# SafeRoute — Clean Continuation Notebook

This notebook replaces the 350+ cell exploratory notebook with a small, restart-friendly pipeline.

## Run order

1. Mount Drive + load data
2. Install/import required packages
3. Build/load cached Chennai OSM road network
4. Build/load crime → OSM risk layer
5. Build environment fuzzy risk and map it to OSM
6. Build/load infrastructure features
7. Calculate infrastructure fuzzy risk **vectorized** (no 174k-row fuzzy loop)
8. Combine static road risk
9. Generate diverse candidate routes
10. Score routes using current static risk

The expensive spatial products are cached to Google Drive so a future Colab restart does not require recomputing them.

**Do not use the old per-row `ControlSystemSimulation` infrastructure cell.**

In [ ]:
from google.colab import drive
drive.mount("/content/drive")

Mounted at /content/drive


In [ ]:
# Install only what this clean notebook needs.
# If Colab already has the packages, this finishes quickly.

!pip -q install osmnx geopandas shapely networkx scikit-fuzzy pyogrio

   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 104.7/104.7 kB 5.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 920.8/920.8 kB 35.7 MB/s eta 0:00:00


In [ ]:
import os
import pickle
import numpy as np
import pandas as pd
import geopandas as gpd
import networkx as nx
import osmnx as ox
import skfuzzy as fuzz
from skfuzzy import control as ctrl

DATA_DIR = "/content/drive/MyDrive/chennai_safe_route_dataset"
CACHE_DIR = os.path.join(DATA_DIR, "_saferoute_cache")
os.makedirs(CACHE_DIR, exist_ok=True)

print("Data directory:", DATA_DIR)
print("Cache directory:", CACHE_DIR)

# Development datasets
crime_df = pd.read_csv(os.path.join(DATA_DIR, "02_crime_incidents.csv"))
roads = pd.read_csv(os.path.join(DATA_DIR, "03_road_segments.csv"))
environment_df = pd.read_csv(os.path.join(DATA_DIR, "04_road_environment.csv"))
infrastructure_df = pd.read_csv(os.path.join(DATA_DIR, "05_safety_pois.csv"))

print("Crime:", crime_df.shape)
print("Road/environment:", roads.shape, environment_df.shape)
print("POIs:", infrastructure_df.shape)

Data directory: /content/drive/MyDrive/chennai_safe_route_dataset
Cache directory: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache
Crime: (8500, 14)
Road/environment: (795, 15) (795, 18)
POIs: (420, 8)


## 1. Load or download the Chennai driving network

The first run may take a few minutes because OSMnx downloads the Chennai road network.

After that, the graph is saved to Drive and future sessions load the cached graph instead.

In [ ]:
GRAPH_CACHE = os.path.join(CACHE_DIR, "chennai_drive.graphml")

if os.path.exists(GRAPH_CACHE):
    print("Loading cached Chennai OSM graph...")
    chennai_graph = ox.load_graphml(GRAPH_CACHE)
else:
    print("Downloading Chennai driving network from OpenStreetMap...")
    chennai_graph = ox.graph_from_place(
        "Chennai, Tamil Nadu, India",
        network_type="drive",
        simplify=True
    )
    ox.save_graphml(chennai_graph, GRAPH_CACHE)
    print("Graph cached:", GRAPH_CACHE)

print("Nodes:", len(chennai_graph.nodes))
print("Edges:", len(chennai_graph.edges))

Loading cached Chennai OSM graph...
Nodes: 68667
Edges: 173935


In [ ]:
# Build the OSM edge/segment master once.

OSM_CACHE = os.path.join(CACHE_DIR, "osm_segments.pkl")

if os.path.exists(OSM_CACHE):
    print("Loading cached OSM segment master...")
    osm_segments_gdf = pd.read_pickle(OSM_CACHE)
    osm_segments_gdf = gpd.GeoDataFrame(
        osm_segments_gdf,
        geometry="geometry",
        crs="EPSG:4326"
    )
else:
    print("Creating OSM segment master...")
    osm_edges = ox.graph_to_gdfs(
        chennai_graph,
        nodes=False,
        edges=True
    ).reset_index()

    osm_edges["osm_segment_id"] = (
        osm_edges["u"].astype(str) + "_" +
        osm_edges["v"].astype(str) + "_" +
        osm_edges["key"].astype(str)
    )

    osm_segments_gdf = osm_edges[
        [
            "osm_segment_id", "u", "v", "key", "osmid",
            "name", "highway", "oneway", "length",
            "lanes", "maxspeed", "bridge", "tunnel",
            "junction", "geometry"
        ]
    ].copy()

    osm_segments_gdf = gpd.GeoDataFrame(
        osm_segments_gdf,
        geometry="geometry",
        crs="EPSG:4326"
    )

    osm_segments_gdf.to_pickle(OSM_CACHE)

print("OSM segments:", len(osm_segments_gdf))

projected_crs = ox.projection.project_gdf(osm_segments_gdf).crs
osm_projected = osm_segments_gdf.to_crs(projected_crs)

print("Projected CRS:", projected_crs)

Loading cached OSM segment master...
OSM segments: 173935
Projected CRS: EPSG:32644


## 2. Crime → OSM risk layer

This reproduces the final crime spatial layer already established in the original notebook.

The crime records are synthetic development data. The resulting `crime_risk_100` is a **relative crime intensity index**, not a probability.

In [ ]:
CRIME_CACHE = os.path.join(CACHE_DIR, "osm_crime_features.pkl")

if os.path.exists(CRIME_CACHE):
    print("Loading cached crime risk layer...")
    osm_crime_features = pd.read_pickle(CRIME_CACHE)
    osm_crime_features = gpd.GeoDataFrame(
        osm_crime_features,
        geometry="geometry",
        crs=projected_crs
    )
else:
    print("Building crime → OSM mapping...")

    crime_df["latitude"] = pd.to_numeric(crime_df["latitude"], errors="coerce")
    crime_df["longitude"] = pd.to_numeric(crime_df["longitude"], errors="coerce")

    crime_df["incident_date"] = pd.to_datetime(
        crime_df["incident_date"],
        errors="coerce"
    )

    crime_gdf = gpd.GeoDataFrame(
        crime_df.copy(),
        geometry=gpd.points_from_xy(
            crime_df["longitude"],
            crime_df["latitude"]
        ),
        crs="EPSG:4326"
    ).to_crs(projected_crs)

    crime_to_road = gpd.sjoin_nearest(
        crime_gdf,
        osm_projected[["osm_segment_id", "name", "geometry"]],
        how="left",
        max_distance=100,
        distance_col="distance_to_road_m"
    )

    crime_to_road_unique = (
        crime_to_road
        .sort_values("distance_to_road_m")
        .drop_duplicates("incident_id", keep="first")
        .copy()
    )

    print(
        "Matched:",
        crime_to_road_unique["osm_segment_id"].notna().sum(),
        "/",
        len(crime_df)
    )

    # Historical crime by OSM segment.
    historical = (
        crime_to_road_unique
        .dropna(subset=["osm_segment_id"])
        .groupby("osm_segment_id")
        .agg(
            historical_crime_count=("incident_id", "count"),
            historical_high_count=("severity", lambda x: (x == "High").sum()),
            historical_medium_count=("severity", lambda x: (x == "Medium").sum()),
            historical_low_count=("severity", lambda x: (x == "Low").sum()),
            historical_critical_count=("severity", lambda x: (x == "Critical").sum())
        )
        .reset_index()
    )

    # Temporal crime up to the current India-time development cutoff.
    cutoff = pd.Timestamp.now(tz="Asia/Kolkata").tz_localize(None)

    dated = crime_to_road_unique[
        crime_to_road_unique["incident_date"].notna()
    ].copy()

    dated["incident_datetime"] = pd.to_datetime(
        dated["incident_date"].dt.strftime("%Y-%m-%d")
        + " "
        + dated["incident_time"].astype(str),
        format="%Y-%m-%d %H:%M",
        errors="coerce"
    )

    dated = dated[
        dated["incident_datetime"].notna()
        & (dated["incident_datetime"] <= cutoff)
    ].copy()

    def window_features(days):
        start = cutoff - pd.Timedelta(days=days)
        x = dated[dated["incident_datetime"] >= start]

        grouped = (
            x.groupby("osm_segment_id")
             .agg(
                 crime_count=( "incident_id", "count"),
                 high_count=("severity", lambda s: (s == "High").sum()),
                 medium_count=("severity", lambda s: (s == "Medium").sum()),
                 low_count=("severity", lambda s: (s == "Low").sum()),
                 critical_count=("severity", lambda s: (s == "Critical").sum())
             )
             .reset_index()
        )

        return grouped

    c7 = window_features(7).rename(columns={
        "crime_count": "crime_count_7d",
        "high_count": "high_severity_count_7d",
        "medium_count": "medium_severity_count_7d",
        "low_count": "low_severity_count_7d",
        "critical_count": "critical_severity_count_7d"
    })

    c30 = window_features(30).rename(columns={
        "crime_count": "crime_count_30d",
        "high_count": "high_severity_count_30d",
        "medium_count": "medium_severity_count_30d",
        "low_count": "low_severity_count_30d",
        "critical_count": "critical_severity_count_30d"
    })

    c90 = window_features(90).rename(columns={
        "crime_count": "crime_count_90d",
        "high_count": "high_severity_count_90d",
        "medium_count": "medium_severity_count_90d",
        "low_count": "low_severity_count_90d",
        "critical_count": "critical_severity_count_90d"
    })

    osm_crime_features = osm_projected.copy()

    osm_crime_features = osm_crime_features.merge(
        historical,
        on="osm_segment_id",
        how="left"
    )

    for frame in [c7, c30, c90]:
        osm_crime_features = osm_crime_features.merge(
            frame,
            on="osm_segment_id",
            how="left"
        )

    count_cols = [
        c for c in osm_crime_features.columns
        if c.startswith("historical_")
        or c.startswith("crime_count_")
        or "severity_count_" in c
    ]

    osm_crime_features[count_cols] = (
        osm_crime_features[count_cols].fillna(0)
    )

    # Transparent severity convention established in the project.
    osm_crime_features["historical_severity_score"] = (
        osm_crime_features["historical_critical_count"] * 1.00
        + osm_crime_features["historical_high_count"] * 0.80
        + osm_crime_features["historical_medium_count"] * 0.50
        + osm_crime_features["historical_low_count"] * 0.25
    )

    osm_crime_features["crime_90d_severity_score"] = (
        osm_crime_features["critical_severity_count_90d"] * 1.00
        + osm_crime_features["high_severity_count_90d"] * 0.80
        + osm_crime_features["medium_severity_count_90d"] * 0.50
        + osm_crime_features["low_severity_count_90d"] * 0.25
    )

    # Relative intensity index.
    def normalize_max(s):
        m = s.max()
        return s / m if m > 0 else s * 0

    hist_n = normalize_max(
        osm_crime_features["historical_severity_score"]
    )
    c90_n = normalize_max(
        osm_crime_features["crime_90d_severity_score"]
    )
    c30_n = normalize_max(
        osm_crime_features["crime_count_30d"]
    )
    c7_n = normalize_max(
        osm_crime_features["crime_count_7d"]
    )

    osm_crime_features["crime_risk"] = (
        0.40 * hist_n
        + 0.30 * c90_n
        + 0.20 * c30_n
        + 0.10 * c7_n
    ) * 100

    nonzero = osm_crime_features["crime_risk"] > 0
    p99 = osm_crime_features.loc[
        nonzero, "crime_risk"
    ].quantile(0.99)

    osm_crime_features["crime_risk_100"] = 0.0

    if p99 > 0:
        osm_crime_features.loc[nonzero, "crime_risk_100"] = (
            osm_crime_features.loc[nonzero, "crime_risk"]
            / p99 * 100
        ).clip(upper=100)

    bins = [-0.01, 20, 40, 60, 80, 100]
    labels = ["Very Low", "Low", "Moderate", "High", "Very High"]

    osm_crime_features["crime_risk_level"] = pd.cut(
        osm_crime_features["crime_risk_100"],
        bins=bins,
        labels=labels
    )

    osm_crime_features.to_pickle(CRIME_CACHE)

print(
    osm_crime_features[
        ["osm_segment_id", "name", "crime_risk_100", "crime_risk_level"]
    ]["crime_risk_100"].describe()
)

Loading cached crime risk layer...
count    173935.000000
mean          0.199503
std           2.560409
min           0.000000
25%           0.000000
50%           0.000000
75%           0.000000
max         100.000000
Name: crime_risk_100, dtype: float64


## 3. Environment fuzzy risk

The original environment data has 795 synthetic development road segments and 8 rows without a fuzzy result.

We keep those 8 as missing, as previously decided.

The fuzzy calculation below is vectorized; there is no 795-row `ControlSystemSimulation` loop.

In [ ]:
def trapmf_np(x, a, b, c, d):
    x = np.asarray(x, dtype=float)

    left = np.where(
        b != a,
        (x - a) / (b - a),
        np.where(x >= b, 1.0, 0.0)
    )

    right = np.where(
        d != c,
        (d - x) / (d - c),
        np.where(x <= c, 1.0, 0.0)
    )

    return np.clip(np.minimum(left, right), 0, 1)


def trimf_np(x, a, b, c):
    x = np.asarray(x, dtype=float)

    left = np.where(
        b != a,
        (x - a) / (b - a),
        np.where(x >= b, 1.0, 0.0)
    )

    right = np.where(
        c != b,
        (c - x) / (c - b),
        np.where(x <= b, 1.0, 0.0)
    )

    return np.clip(np.minimum(left, right), 0, 1)


def centroid_from_three_outputs(low_strength, medium_strength, high_strength):
    x = np.linspace(0, 100, 1001)

    low = trimf_np(x, 0, 0, 35)
    medium = trimf_np(x, 20, 50, 75)
    high = trimf_np(x, 60, 100, 100)

    # Process in chunks to keep memory small.
    out = np.full(len(low_strength), np.nan)

    for start in range(0, len(out), 20000):
        end = min(start + 20000, len(out))

        a = np.minimum(low[None, :], low_strength[start:end, None])
        b = np.minimum(medium[None, :], medium_strength[start:end, None])
        c = np.minimum(high[None, :], high_strength[start:end, None])

        agg = np.maximum.reduce([a, b, c])

        den = agg.sum(axis=1)
        num = (agg * x[None, :]).sum(axis=1)

        out[start:end] = np.divide(
            num,
            den,
            out=np.full(end - start, np.nan),
            where=den > 0
        )

    return out


e = environment_df.copy()

lighting = e["lighting_score"].to_numpy(float)
visibility = e["visibility_score"].to_numpy(float)
isolation = e["isolation_score"].to_numpy(float)
pedestrian = e["pedestrian_score"].to_numpy(float)
crowd = e["crowd_score"].to_numpy(float)
sidewalk = e["sidewalk_score"].to_numpy(float)
road_condition = e["road_condition_score"].to_numpy(float)

# Membership functions
lighting_poor = trapmf_np(lighting, 0, 0, .25, .45)
lighting_mod = trimf_np(lighting, .30, .55, .75)
lighting_good = trapmf_np(lighting, .60, .80, 1, 1)

visibility_poor = trapmf_np(visibility, 0, 0, .25, .45)
visibility_mod = trimf_np(visibility, .30, .55, .75)
visibility_good = trapmf_np(visibility, .60, .80, 1, 1)

isolation_low = trapmf_np(isolation, 0, 0, .25, .40)
isolation_med = trimf_np(isolation, .25, .50, .70)
isolation_high = trapmf_np(isolation, .55, .75, 1, 1)

ped_low = trapmf_np(pedestrian, 0, 0, .25, .45)
ped_med = trimf_np(pedestrian, .30, .55, .75)
ped_high = trapmf_np(pedestrian, .60, .80, 1, 1)

crowd_low = trapmf_np(crowd, 0, 0, .25, .45)
crowd_med = trimf_np(crowd, .30, .55, .75)
crowd_high = trapmf_np(crowd, .60, .80, 1, 1)

sidewalk_poor = trapmf_np(sidewalk, 0, 0, .25, .45)
sidewalk_mod = trimf_np(sidewalk, .30, .55, .75)
sidewalk_good = trapmf_np(sidewalk, .60, .80, 1, 1)

road_poor = trapmf_np(road_condition, 0, 0, .25, .45)
road_mod = trimf_np(road_condition, .30, .55, .75)
road_good = trapmf_np(road_condition, .60, .80, 1, 1)

# Rules from the original notebook.
high_rules = [
    np.minimum(lighting_poor, visibility_poor),
    np.minimum(lighting_poor, isolation_high),
    np.minimum(isolation_high, ped_low),
    np.minimum(isolation_high, crowd_low),
    np.minimum(sidewalk_poor, road_poor),
    np.minimum(visibility_poor, ped_low),
]

medium_rules = [
    np.minimum(lighting_mod, visibility_mod),
    np.minimum(isolation_med, ped_med),
    np.minimum(crowd_med, sidewalk_mod),
    np.minimum(road_mod, visibility_mod),
]

low_rules = [
    np.minimum.reduce([lighting_good, visibility_good, isolation_low, crowd_high]),
    np.minimum.reduce([lighting_good, sidewalk_good, road_good]),
]

environment_high = np.maximum.reduce(high_rules)
environment_medium = np.maximum.reduce(medium_rules)
environment_low = np.maximum.reduce(low_rules)

environment_df["environment_risk_100"] = centroid_from_three_outputs(
    environment_low,
    environment_medium,
    environment_high
)

print(
    "Calculated:",
    environment_df["environment_risk_100"].notna().sum()
)
print(
    "Missing:",
    environment_df["environment_risk_100"].isna().sum()
)
display(environment_df["environment_risk_100"].describe())

Calculated: 787
Missing: 8


/tmp/ipykernel_3386/1818519090.py:6: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:12: RuntimeWarning: divide by zero encountered in divide
  (d - x) / (d - c),
/tmp/ipykernel_3386/1818519090.py:12: RuntimeWarning: invalid value encountered in divide
  (d - x) / (d - c),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: invalid value encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: divide by zero encountered in divide
  (c - x) / (c - b),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: invalid value encountered in divide
  (c - x) / (c - b),


,environment_risk_100
count,787.000000
mean,48.725929
std,12.196258
min,11.633333
25%,47.667544
50%,48.181855
75%,48.322439
max,86.700000


## 4. Map environment data onto the actual OSM road network

The synthetic environment IDs (`SEG0001`, etc.) are not OSM IDs, so we do **not** directly join them.

Instead, the synthetic road geometries are matched to the nearest OSM road segment.

This creates an explicit bridge between the development environment layer and the actual routing network.

In [ ]:
ENV_OSM_CACHE = os.path.join(CACHE_DIR, "osm_environment_features.pkl")

if os.path.exists(ENV_OSM_CACHE):
    print("Loading cached OSM environment layer...")
    osm_environment_features = pd.read_pickle(ENV_OSM_CACHE)
    osm_environment_features = gpd.GeoDataFrame(
        osm_environment_features,
        geometry="geometry",
        crs=projected_crs
    )
else:
    road_gdf = gpd.GeoDataFrame(
        roads.copy(),
        geometry=gpd.GeoSeries.from_wkt(roads["geometry"]),
        crs="EPSG:4326"
    ).to_crs(projected_crs)

    env_for_join = road_gdf[
        ["segment_id", "geometry"]
    ].merge(
        environment_df[
            [
                "segment_id",
                "environment_risk_100"
            ]
        ],
        on="segment_id",
        how="left"
    )

    env_to_osm = gpd.sjoin_nearest(
        env_for_join,
        osm_projected[
            ["osm_segment_id", "geometry"]
        ],
        how="left",
        max_distance=150,
        distance_col="environment_match_m"
    )

    env_to_osm = (
        env_to_osm
        .sort_values("environment_match_m")
        .drop_duplicates("segment_id")
    )

    osm_environment_features = osm_projected[
        ["osm_segment_id", "geometry"]
    ].copy()

    osm_environment_features = osm_environment_features.merge(
        env_to_osm[
            [
                "osm_segment_id",
                "environment_risk_100",
                "environment_match_m"
            ]
        ],
        on="osm_segment_id",
        how="left"
    )

    osm_environment_features.to_pickle(ENV_OSM_CACHE)

print(
    "OSM environment coverage:",
    osm_environment_features["environment_risk_100"].notna().sum(),
    "/",
    len(osm_environment_features)
)

print(
    "Missing environment on OSM:",
    osm_environment_features["environment_risk_100"].isna().sum()
)

Loading cached OSM environment layer...
OSM environment coverage: 659 / 173954
Missing environment on OSM: 173295


In [ ]:
# Recreate env_to_osm mapping from the original spatial join logic.
# This does NOT recompute environment risk.

road_gdf = gpd.GeoDataFrame(
    roads.copy(),
    geometry=gpd.GeoSeries.from_wkt(roads["geometry"]),
    crs="EPSG:4326"
).to_crs(projected_crs)

env_for_join = road_gdf[
    ["segment_id", "geometry"]
].merge(
    environment_df[
        [
            "segment_id",
            "environment_risk_100"
        ]
    ],
    on="segment_id",
    how="left"
)

env_to_osm = gpd.sjoin_nearest(
    env_for_join,
    osm_projected[
        ["osm_segment_id", "geometry"]
    ],
    how="left",
    max_distance=150,
    distance_col="environment_match_m"
)

env_to_osm = (
    env_to_osm
    .sort_values("environment_match_m")
    .drop_duplicates("segment_id")
)

print("env_to_osm shape:", env_to_osm.shape)
print(
    env_to_osm[
        ["segment_id", "osm_segment_id", "environment_risk_100",
         "environment_match_m"]
    ].head()
)

env_to_osm shape: (795, 6)
    segment_id           osm_segment_id  environment_risk_100  \
513    SEG0514    291994302_291992663_0             48.171932   
515    SEG0516  2174395090_2174395075_0             46.269057   
514    SEG0515    388126070_388126071_0             48.233551   
516    SEG0517    388130998_388130997_0             54.553364   
518    SEG0519  300218566_11601259159_0             13.278307   

     environment_match_m  
513                  0.0  
515                  0.0  
514                  0.0  
516                  0.0  
518                  0.0  


In [ ]:
print("Unique environment segments:",
      env_to_osm["segment_id"].nunique())

print("Unique OSM segments:",
      env_to_osm["osm_segment_id"].nunique())

print("Missing OSM mapping:",
      env_to_osm["osm_segment_id"].isna().sum())

Unique environment segments: 795
Unique OSM segments: 647
Missing OSM mapping: 129


## 5. Infrastructure features

POIs are mapped to all OSM road segments using projected spatial joins.

These are the six features already established in the original notebook.

In [ ]:
INFRA_CACHE = os.path.join(CACHE_DIR, "infra_features_osm.pkl")

if os.path.exists(INFRA_CACHE):
    print("Loading cached infrastructure features...")
    infra_features_osm = pd.read_pickle(INFRA_CACHE)
    infra_features_osm = gpd.GeoDataFrame(
        infra_features_osm,
        geometry="geometry",
        crs=projected_crs
    )
else:
    poi_gdf = gpd.GeoDataFrame(
        infrastructure_df.copy(),
        geometry=gpd.points_from_xy(
            infrastructure_df["longitude"],
            infrastructure_df["latitude"]
        ),
        crs="EPSG:4326"
    ).to_crs(projected_crs)

    police_pois = poi_gdf[
        poi_gdf["poi_type"].isin(
            ["POLICE_STATION", "POLICE_BOOTH"]
        )
    ].copy()

    hospital_pois = poi_gdf[
        poi_gdf["poi_type"] == "HOSPITAL"
    ].copy()

    metro_pois = poi_gdf[
        poi_gdf["poi_type"] == "METRO_STATION"
    ].copy()

    bus_pois = poi_gdf[
        poi_gdf["poi_type"] == "BUS_STOP"
    ].copy()

    cctv_pois = poi_gdf[
        poi_gdf["poi_type"] == "CCTV"
    ].copy()

    def nearest_distance_km(roads_gdf, pois):
        joined = gpd.sjoin_nearest(
            roads_gdf[["osm_segment_id", "geometry"]],
            pois[["geometry"]],
            how="left",
            distance_col="distance_m"
        )

        joined = (
            joined
            .sort_values("distance_m")
            .drop_duplicates("osm_segment_id")
        )

        return (
            joined
            .set_index("osm_segment_id")["distance_m"]
            .reindex(roads_gdf["osm_segment_id"])
            .to_numpy() / 1000.0
        )

    def count_pois_within_radius(roads_gdf, pois, radius_m=500):
        joined = gpd.sjoin(
            roads_gdf[["osm_segment_id", "geometry"]],
            pois[["geometry"]],
            how="left",
            predicate="dwithin",
            distance=radius_m
        )

        counts = joined.groupby("osm_segment_id").size()

        return (
            roads_gdf["osm_segment_id"]
            .map(counts)
            .fillna(0)
            .astype(int)
            .to_numpy()
        )

    infra_features_osm = osm_projected[
        ["osm_segment_id", "geometry"]
    ].copy()

    infra_features_osm["police_distance_km"] = nearest_distance_km(
        infra_features_osm, police_pois
    )

    infra_features_osm["hospital_distance_km"] = nearest_distance_km(
        infra_features_osm, hospital_pois
    )

    infra_features_osm["metro_distance_km"] = nearest_distance_km(
        infra_features_osm, metro_pois
    )

    infra_features_osm["bus_stop_distance_km"] = nearest_distance_km(
        infra_features_osm, bus_pois
    )

    infra_features_osm["police_points_500m"] = count_pois_within_radius(
        infra_features_osm, police_pois, 500
    )

    infra_features_osm["cctv_count_500m"] = count_pois_within_radius(
        infra_features_osm, cctv_pois, 500
    )

    infra_features_osm.to_pickle(INFRA_CACHE)

infra_cols = [
    "police_distance_km",
    "hospital_distance_km",
    "metro_distance_km",
    "bus_stop_distance_km",
    "police_points_500m",
    "cctv_count_500m"
]

print("Infrastructure rows:", len(infra_features_osm))
display(infra_features_osm[infra_cols].describe().T)
print("Missing:")
display(infra_features_osm[infra_cols].isna().sum())

Loading cached infrastructure features...
Infrastructure rows: 173935


,count,mean,std,min,25%,50%,75%,max
police_distance_km,173935.0,2.026977,1.215495,0.000497,1.166587,1.859006,2.611555,7.631097
hospital_distance_km,173935.0,3.516645,1.869639,0.001213,2.024535,3.308654,4.729206,9.117437
metro_distance_km,173935.0,2.290225,1.290007,0.001609,1.288664,2.112478,3.155158,7.660013
bus_stop_distance_km,173935.0,1.217481,0.860934,0.000343,0.591249,1.028922,1.649066,6.757431
police_points_500m,173935.0,1.006681,0.082165,1.000000,1.000000,1.000000,1.000000,3.000000
cctv_count_500m,173935.0,1.051330,0.276750,1.000000,1.000000,1.000000,1.000000,5.000000


Missing:


,0
police_distance_km,0
hospital_distance_km,0
metro_distance_km,0
bus_stop_distance_km,0
police_points_500m,0
cctv_count_500m,0


## 6. Infrastructure fuzzy risk — vectorized

This replaces the old 174,014-row `ControlSystemSimulation` loop.

The fuzzy rules and membership functions are the same ones already validated:

- Good infrastructure ≈ 13.61 risk
- Poor infrastructure ≈ 86.67 risk

In [ ]:
# Reuse the vectorized membership helpers.

df = infra_features_osm.copy()

pd_km = df["police_distance_km"].to_numpy(float)
hd_km = df["hospital_distance_km"].to_numpy(float)
md_km = df["metro_distance_km"].to_numpy(float)
bd_km = df["bus_stop_distance_km"].to_numpy(float)
pp = df["police_points_500m"].to_numpy(float)
cctv = df["cctv_count_500m"].to_numpy(float)

# Input membership functions
pd_near = trapmf_np(pd_km, 0, 0, .8, 1.5)
pd_medium = trimf_np(pd_km, 1, 2.5, 4)
pd_far = trapmf_np(pd_km, 3, 4.5, 8, 8)

hd_near = trapmf_np(hd_km, 0, 0, 1.2, 2.2)
hd_medium = trimf_np(hd_km, 1.5, 3.5, 5.5)
hd_far = trapmf_np(hd_km, 4.5, 6, 10, 10)

md_near = trapmf_np(md_km, 0, 0, .8, 1.5)
md_medium = trimf_np(md_km, 1, 2.5, 4)
md_far = trapmf_np(md_km, 3, 4.5, 8, 8)

bd_near = trapmf_np(bd_km, 0, 0, .3, .7)
bd_medium = trimf_np(bd_km, .5, 1.2, 2)
bd_far = trapmf_np(bd_km, 1.5, 2.5, 7, 7)

pp_low = trapmf_np(pp, 0, 0, 1, 1.5)
pp_medium = trimf_np(pp, 1, 1.5, 2)
pp_high = trapmf_np(pp, 1.5, 2, 3, 3)

cctv_low = trapmf_np(cctv, 0, 0, 1, 1.5)
cctv_medium = trimf_np(cctv, 1, 2, 3)
cctv_high = trapmf_np(cctv, 2.5, 3.5, 5, 5)

# Rules
r1 = np.minimum(pd_far, hd_far)
r2 = np.minimum(pd_far, pp_low)
r3 = np.minimum(pd_far, cctv_low)
r4 = np.minimum(hd_far, cctv_low)
r5 = np.minimum(md_far, bd_far)

r6 = np.minimum(pd_medium, hd_medium)
r7 = np.minimum(pd_medium, pp_medium)
r8 = np.minimum(hd_medium, cctv_medium)
r9 = np.minimum(md_medium, bd_medium)

r10 = np.minimum.reduce([pd_near, pp_high, cctv_high])
r11 = np.minimum.reduce([pd_near, hd_near, cctv_high])
r12 = np.minimum.reduce([bd_near, md_near, cctv_high])

high_strength = np.maximum.reduce([r1, r2, r3, r4, r5])
medium_strength = np.maximum.reduce([r6, r7, r8, r9])
low_strength = np.maximum.reduce([r10, r11, r12])

df["infrastructure_risk_100"] = centroid_from_three_outputs(
    low_strength,
    medium_strength,
    high_strength
)

infra_features_osm = df

print(
    "Calculated:",
    infra_features_osm["infrastructure_risk_100"].notna().sum()
)
print(
    "Missing:",
    infra_features_osm["infrastructure_risk_100"].isna().sum()
)
display(infra_features_osm["infrastructure_risk_100"].describe())

/tmp/ipykernel_3386/1818519090.py:6: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:12: RuntimeWarning: divide by zero encountered in divide
  (d - x) / (d - c),
/tmp/ipykernel_3386/1818519090.py:12: RuntimeWarning: invalid value encountered in divide
  (d - x) / (d - c),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: invalid value encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: divide by zero encountered in divide
  (c - x) / (c - b),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: invalid value encountered in divide
  (c - x) / (c - b),


Calculated: 154043
Missing: 19892


,infrastructure_risk_100
count,154043.000000
mean,59.103851
std,14.941224
min,11.633333
25%,47.938857
50%,48.291335
75%,69.194763
max,86.700000


In [ ]:
# Validate the vectorized infrastructure implementation
# against the two scenarios already validated with scikit-fuzzy.

def scalar_infra_check(
    police, hospital, metro, bus, police_points, cctv
):
    p_n = trapmf_np(np.array([police]), 0, 0, .8, 1.5)[0]
    p_m = trimf_np(np.array([police]), 1, 2.5, 4)[0]
    p_f = trapmf_np(np.array([police]), 3, 4.5, 8, 8)[0]

    h_n = trapmf_np(np.array([hospital]), 0, 0, 1.2, 2.2)[0]
    h_m = trimf_np(np.array([hospital]), 1.5, 3.5, 5.5)[0]
    h_f = trapmf_np(np.array([hospital]), 4.5, 6, 10, 10)[0]

    m_n = trapmf_np(np.array([metro]), 0, 0, .8, 1.5)[0]
    m_m = trimf_np(np.array([metro]), 1, 2.5, 4)[0]
    m_f = trapmf_np(np.array([metro]), 3, 4.5, 8, 8)[0]

    b_n = trapmf_np(np.array([bus]), 0, 0, .3, .7)[0]
    b_m = trimf_np(np.array([bus]), .5, 1.2, 2)[0]
    b_f = trapmf_np(np.array([bus]), 1.5, 2.5, 7, 7)[0]

    pp_l = trapmf_np(np.array([police_points]), 0, 0, 1, 1.5)[0]
    pp_m = trimf_np(np.array([police_points]), 1, 1.5, 2)[0]
    pp_h = trapmf_np(np.array([police_points]), 1.5, 2, 3, 3)[0]

    c_l = trapmf_np(np.array([cctv]), 0, 0, 1, 1.5)[0]
    c_m = trimf_np(np.array([cctv]), 1, 2, 3)[0]
    c_h = trapmf_np(np.array([cctv]), 2.5, 3.5, 5, 5)[0]

    hi = max(
        min(p_f, h_f),
        min(p_f, pp_l),
        min(p_f, c_l),
        min(h_f, c_l),
        min(m_f, b_f)
    )

    me = max(
        min(p_m, h_m),
        min(p_m, pp_m),
        min(h_m, c_m),
        min(m_m, b_m)
    )

    lo = max(
        min(p_n, pp_h, c_h),
        min(p_n, h_n, c_h),
        min(b_n, m_n, c_h)
    )

    return centroid_from_three_outputs(
        np.array([lo]),
        np.array([me]),
        np.array([hi])
    )[0]


print(
    "Good scenario:",
    scalar_infra_check(.5, 1.0, .5, .2, 2, 3)
)

print(
    "Poor scenario:",
    scalar_infra_check(5, 7, 5, 2, 0, 0)
)

Good scenario: 13.585171102661596
Poor scenario: 86.7


/tmp/ipykernel_3386/1818519090.py:6: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:12: RuntimeWarning: divide by zero encountered in divide
  (d - x) / (d - c),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: divide by zero encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:24: RuntimeWarning: invalid value encountered in divide
  (x - a) / (b - a),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: divide by zero encountered in divide
  (c - x) / (c - b),
/tmp/ipykernel_3386/1818519090.py:30: RuntimeWarning: invalid value encountered in divide
  (c - x) / (c - b),
/tmp/ipykernel_3386/1818519090.py:6: RuntimeWarning: invalid value encountered in divide
  (x - a) / (b - a),


## 7. Combine the three static layers

For this prototype we use the **mean of available component risks** rather than inventing fixed weights.

Later, the ML/validation stage can learn the fusion weights.

Missing environment values remain missing at the component level. The combined score uses whichever static components are available.

In [ ]:
STATIC_CACHE = os.path.join(CACHE_DIR, "osm_static_risk.pkl")

static_risk = osm_crime_features[
    ["osm_segment_id", "geometry", "length", "name", "highway",
     "crime_risk_100"]
].copy()

static_risk = static_risk.merge(
    osm_environment_features[
        ["osm_segment_id", "environment_risk_100"]
    ],
    on="osm_segment_id",
    how="left"
)

static_risk = static_risk.merge(
    infra_features_osm[
        ["osm_segment_id", "infrastructure_risk_100"]
    ],
    on="osm_segment_id",
    how="left"
)

component_cols = [
    "crime_risk_100",
    "environment_risk_100",
    "infrastructure_risk_100"
]

static_risk["static_risk_100"] = (
    static_risk[component_cols].mean(axis=1, skipna=True)
)

static_risk["static_components_available"] = (
    static_risk[component_cols].notna().sum(axis=1)
)

static_risk["static_safety_score"] = (
    100 - static_risk["static_risk_100"]
).clip(0, 100)

static_risk.to_pickle(STATIC_CACHE)

print("Static road layer:", static_risk.shape)
display(
    static_risk[
        component_cols
        + ["static_risk_100", "static_components_available"]
    ].describe()
)

Static road layer: (173954, 11)


,crime_risk_100,environment_risk_100,infrastructure_risk_100,static_risk_100,static_components_available
count,173954.000000,659.000000,154051.000000,173954.000000,173954.000000
mean,0.205124,48.734743,59.103535,26.332116,1.889373
std,2.652117,12.258958,14.941088,11.766153,0.322651
min,0.000000,11.633333,11.633333,0.000000,1.000000
25%,0.000000,47.620832,47.938800,23.902849,2.000000
50%,0.000000,48.180853,48.291335,24.114052,2.000000
75%,0.000000,48.321372,69.194369,33.568504,2.000000
max,100.000000,86.700000,86.700000,100.000000,3.000000


## 8. Candidate route generation + static scoring

This is the first complete routing prototype.

It generates up to 20 candidates, removes near-duplicates using Jaccard similarity, and scores the remaining routes by length-weighted static risk.

It does **not** yet include live traffic/weather or Google navigation instructions.

In [ ]:
from itertools import islice

SOURCE = (13.0827, 80.2707)       # Chennai Central
DESTINATION = (13.0500, 80.2824)  # Marina Beach

source_node = ox.distance.nearest_nodes(
    chennai_graph,
    X=SOURCE[1],
    Y=SOURCE[0]
)

dest_node = ox.distance.nearest_nodes(
    chennai_graph,
    X=DESTINATION[1],
    Y=DESTINATION[0]
)

candidate_routes = list(
    islice(
        ox.routing.k_shortest_paths(
            chennai_graph,
            source_node,
            dest_node,
            k=20,
            weight="length"
        ),
        20
    )
)

print("Candidate routes:", len(candidate_routes))

def route_edges(graph, route):
    records = []

    for u, v in zip(route[:-1], route[1:]):
        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        records.append((u, v, key))

    return records


def route_segment_ids(route):
    return [
        f"{u}_{v}_{key}"
        for u, v, key in route_edges(
            chennai_graph,
            route
        )
    ]


route_sets = [
    set(route_segment_ids(r))
    for r in candidate_routes
]

# Greedy diversity selection.
selected = []

for i, route_set in enumerate(route_sets):
    if not selected:
        selected.append(i)
        continue

    max_similarity = max(
        len(route_set & route_sets[j]) /
        len(route_set | route_sets[j])
        for j in selected
        if len(route_set | route_sets[j]) > 0
    )

    if max_similarity < 0.70:
        selected.append(i)

    if len(selected) == 5:
        break

print("Diverse routes selected:", len(selected))

selected_routes = [
    candidate_routes[i]
    for i in selected
]

Candidate routes: 20
Diverse routes selected: 3


In [ ]:
# Score selected routes using the static road risk layer.

risk_lookup = static_risk.set_index(
    "osm_segment_id"
)["static_risk_100"].to_dict()

length_lookup = static_risk.set_index(
    "osm_segment_id"
)["length"].to_dict()

name_lookup = static_risk.set_index(
    "osm_segment_id"
)["name"].to_dict()

route_results = []

for rank, route in enumerate(selected_routes, start=1):

    segment_ids = route_segment_ids(route)

    rows = []

    for sid in segment_ids:
        if sid not in risk_lookup:
            continue

        rows.append({
            "osm_segment_id": sid,
            "risk": risk_lookup[sid],
            "length_m": length_lookup.get(sid, 0),
            "road_name": name_lookup.get(sid, "Unnamed Road")
        })

    route_df = pd.DataFrame(rows)

    if route_df.empty:
        continue

    total_length = route_df["length_m"].sum()

    weighted_risk = (
        (route_df["risk"] * route_df["length_m"]).sum()
        / total_length
        if total_length > 0
        else np.nan
    )

    route_results.append({
        "rank": rank,
        "segments": len(segment_ids),
        "mapped_segments": len(route_df),
        "distance_km": total_length / 1000,
        "static_risk_100": weighted_risk,
        "static_safety_score": 100 - weighted_risk
    })

route_results_df = pd.DataFrame(route_results)

display(
    route_results_df.sort_values(
        "static_safety_score",
        ascending=False
    )
)

,rank,segments,mapped_segments,distance_km,static_risk_100,static_safety_score
1,2,88,88,5.558704,35.105479,64.894521
2,3,95,95,5.571863,35.120066,64.879934
0,1,36,36,5.390545,39.707691,60.292309


# Current stopping point

At this point the clean notebook has reconstructed the work needed for the current stage:

- Chennai OSM road network
- Crime risk on OSM segments
- Environment fuzzy risk + OSM mapping
- Infrastructure features
- Vectorized infrastructure fuzzy risk
- Combined static risk
- Candidate route generation
- Static route scoring

## Next notebook stage

The next cells we add should handle:

1. **Live/request-time traffic**
2. **Live/request-time weather**
3. Departure-time context
4. Dynamic fuzzy risk
5. LightGBM inference at request time
6. Hybrid contextual risk
7. Top-5 route ranking
8. Turn-by-turn road/maneuver output
9. Google Routes/Maps integration
10. Quantum-inspired optimization

Do not add those until this clean static pipeline runs successfully.

# **Stage 2: Dynamic features + LightGBM inference**

In [ ]:
!pip -q install lightgbm

In [ ]:
import os
import numpy as np
import pandas as pd
import geopandas as gpd
import lightgbm as lgb

from pathlib import Path
from datetime import datetime

print("LightGBM:", lgb.__version__)

LightGBM: 4.6.0


In [ ]:
CACHE_DIR = Path(DATA_DIR) / "_saferoute_cache"

osm_segments_gdf = pd.read_pickle(
    CACHE_DIR / "osm_segments.pkl"
)

osm_crime_features = pd.read_pickle(
    CACHE_DIR / "osm_crime_features.pkl"
)

osm_environment_features = pd.read_pickle(
    CACHE_DIR / "osm_environment_features.pkl"
)

infra_features_osm = pd.read_pickle(
    CACHE_DIR / "infra_features_osm.pkl"
)

# Restore GeoDataFrame types if needed
def ensure_geodataframe(df):
    if isinstance(df, gpd.GeoDataFrame):
        return df

    if "geometry" in df.columns:
        return gpd.GeoDataFrame(
            df,
            geometry="geometry",
            crs=getattr(df, "crs", None) or "EPSG:4326"
        )

    return df


osm_segments_gdf = ensure_geodataframe(osm_segments_gdf)
osm_crime_features = ensure_geodataframe(osm_crime_features)
osm_environment_features = ensure_geodataframe(osm_environment_features)
infra_features_osm = ensure_geodataframe(infra_features_osm)

print("OSM segments:", len(osm_segments_gdf))
print("Crime:", len(osm_crime_features))
print("Environment:", len(osm_environment_features))
print("Infrastructure:", len(infra_features_osm))

print("\nTypes:")
print(type(osm_segments_gdf))
print(type(osm_crime_features))
print(type(osm_environment_features))
print(type(infra_features_osm))

OSM segments: 173935
Crime: 173935
Environment: 173954
Infrastructure: 173935

Types:
<class 'geopandas.geodataframe.GeoDataFrame'>
<class 'geopandas.geodataframe.GeoDataFrame'>
<class 'geopandas.geodataframe.GeoDataFrame'>
<class 'geopandas.geodataframe.GeoDataFrame'>


In [ ]:
from pathlib import Path

DATA_DIR = Path(DATA_DIR)

training_path = DATA_DIR / "08_segment_context_training.csv"

training = pd.read_csv(training_path)

print("Training shape:", training.shape)
print("\nColumns:")
print(training.columns.tolist())

Training shape: (279840, 49)

Columns:
['segment_id', 'timestamp', 'hour', 'day_of_week', 'is_weekend', 'is_night', 'hour_sin', 'hour_cos', 'crime_count_7d', 'crime_count_30d', 'crime_count_90d', 'weighted_crime_score', 'high_severity_count', 'medium_severity_count', 'low_severity_count', 'lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'shops_open', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'cctv_count_500m', 'police_points_500m', 'traffic_speed_kmph', 'free_flow_speed_kmph', 'congestion_ratio', 'travel_time_min', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover', 'visibility_km', 'city_complaint_context_score', 'fuzzy_crime_risk', 'fuzzy_environment_risk', 'fuzzy_dynamic_risk', 'fuzzy_infrastructure_risk', 'target_risk_score', 'safety_score', 'risk_level', 'split', 'data_source']


In [ ]:
crime_features = [
    "crime_count_7d",
    "crime_count_30d",
    "crime_count_90d",
    "high_severity_count",
    "medium_severity_count",
    "low_severity_count",
    "weighted_crime_score",
]

environment_features = [
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score",
]

infrastructure_features = [
    "police_distance_km",
    "hospital_distance_km",
    "metro_distance_km",
    "bus_stop_distance_km",
    "police_points_500m",
    "cctv_count_500m",
]

traffic_features = [
    "traffic_speed_kmph",
    "free_flow_speed_kmph",
    "congestion_ratio",
    "travel_time_min",
]

weather_features = [
    "temperature_c",
    "rainfall_mm",
    "humidity",
    "wind_speed_kmh",
    "cloud_cover",
    "visibility_km",
]

time_features = [
    "hour",
    "day_of_week",
    "is_weekend",
    "is_night",
    "hour_sin",
    "hour_cos",
]

ML_FEATURES = (
    crime_features
    + environment_features
    + infrastructure_features
    + traffic_features
    + weather_features
    + time_features
)

print("Total ML features:", len(ML_FEATURES))
print(ML_FEATURES)

Total ML features: 36
['crime_count_7d', 'crime_count_30d', 'crime_count_90d', 'high_severity_count', 'medium_severity_count', 'low_severity_count', 'weighted_crime_score', 'lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'police_points_500m', 'cctv_count_500m', 'traffic_speed_kmph', 'free_flow_speed_kmph', 'congestion_ratio', 'travel_time_min', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover', 'visibility_km', 'hour', 'day_of_week', 'is_weekend', 'is_night', 'hour_sin', 'hour_cos']


In [ ]:
import glob

model_files = []

for pattern in [
    "**/*.pkl",
    "**/*.joblib",
    "**/*.txt",
    "**/*.model",
]:
    model_files.extend(
        glob.glob(str(DATA_DIR / pattern), recursive=True)
    )

lightgbm_candidates = [
    f for f in model_files
    if any(x in Path(f).name.lower()
           for x in ["lightgbm", "lgbm", "lgb", "model"])
]

print("Possible model files:")
for f in lightgbm_candidates[:50]:
    print(f)

Possible model files:
/content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/saferoute_lightgbm.txt
/content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/saferoute_lightgbm_real_weather.txt


In [ ]:
TARGET = "safety_score"

# Verify all required features exist
missing_features = [c for c in ML_FEATURES if c not in training.columns]

print("Missing features:", missing_features)

if missing_features:
    raise ValueError(f"Missing required features: {missing_features}")

X = training[ML_FEATURES].copy()
y = training[TARGET].copy()

print("X shape:", X.shape)
print("y shape:", y.shape)

Missing features: []
X shape: (279840, 36)
y shape: (279840,)


In [ ]:
training["timestamp"] = pd.to_datetime(training["timestamp"], format="%d-%m-%Y %H:%M")

unique_times = sorted(training["timestamp"].unique())

n_times = len(unique_times)

train_end = int(n_times * 0.70)
val_end = int(n_times * 0.85)

train_times = set(unique_times[:train_end])
val_times = set(unique_times[train_end:val_end])
test_times = set(unique_times[val_end:])

train_mask = training["timestamp"].isin(train_times)
val_mask = training["timestamp"].isin(val_times)
test_mask = training["timestamp"].isin(test_times)

X_train = training.loc[train_mask, ML_FEATURES]
y_train = training.loc[train_mask, TARGET]

X_val = training.loc[val_mask, ML_FEATURES]
y_val = training.loc[val_mask, TARGET]

X_test = training.loc[test_mask, ML_FEATURES]
y_test = training.loc[test_mask, TARGET]

print("Train:", X_train.shape)
print("Validation:", X_val.shape)
print("Test:", X_test.shape)

Train: (195570, 36)
Validation: (42135, 36)
Test: (42135, 36)


In [ ]:
import lightgbm as lgb
from sklearn.metrics import mean_absolute_error, mean_squared_error, r2_score
import numpy as np

lgb_model = lgb.LGBMRegressor(
    objective="regression",
    n_estimators=3000,
    learning_rate=0.03,
    num_leaves=31,
    max_depth=-1,
    min_child_samples=30,
    subsample=0.8,
    colsample_bytree=0.8,
    reg_alpha=0.1,
    reg_lambda=0.2,
    random_state=42,
    n_jobs=-1
)

lgb_model.fit(
    X_train,
    y_train,
    eval_set=[(X_val, y_val)],
    eval_metric="rmse",
    callbacks=[
        lgb.early_stopping(
            stopping_rounds=100,
            verbose=True
        )
    ]
)

print("\nBest iteration:", lgb_model.best_iteration_)

[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.113749 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 4363
[LightGBM] [Info] Number of data points in the train set: 195570, number of used features: 36
[LightGBM] [Info] Start training from score 57.462137
Training until validation scores don't improve for 100 rounds
Early stopping, best iteration is:
[1298]	valid_0's rmse: 4.55954	valid_0's l2: 20.7894

Best iteration: 1298


In [ ]:
def evaluate_model(name, model, X, y):
    pred = model.predict(X)

    mae = mean_absolute_error(y, pred)
    rmse = np.sqrt(mean_squared_error(y, pred))
    r2 = r2_score(y, pred)

    print(
        f"{name}: "
        f"MAE={mae:.4f} | "
        f"RMSE={rmse:.4f} | "
        f"R²={r2:.4f}"
    )

    return pred


train_pred = evaluate_model(
    "Train",
    lgb_model,
    X_train,
    y_train
)

val_pred = evaluate_model(
    "Validation",
    lgb_model,
    X_val,
    y_val
)

test_pred = evaluate_model(
    "Test",
    lgb_model,
    X_test,
    y_test
)

Train: MAE=3.4808 | RMSE=4.3673 | R²=0.8678
Validation: MAE=3.6369 | RMSE=4.5595 | R²=0.8636
Test: MAE=3.6727 | RMSE=4.6013 | R²=0.8607


In [ ]:
MODEL_PATH = CACHE_DIR / "saferoute_lightgbm.txt"

lgb_model.booster_.save_model(str(MODEL_PATH))

print("Model saved to:")
print(MODEL_PATH)

Model saved to:
/content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/saferoute_lightgbm.txt


In [ ]:
print("Best iteration:", lgb_model.best_iteration_)
print("Model exists:", MODEL_PATH.exists())
print("Model size:", MODEL_PATH.stat().st_size / (1024 * 1024), "MB")

Best iteration: 1298
Model exists: True
Model size: 3.6298580169677734 MB


# **Stage -2a : real Chennai road inference**

In [ ]:
# Confirm the trained model is available in memory
print("LightGBM model:", type(lgb_model))
print("Best iteration:", lgb_model.best_iteration_)

LightGBM model: <class 'lightgbm.sklearn.LGBMRegressor'>
Best iteration: 1298


In [ ]:
osm_ml = osm_segments_gdf.copy()

print("OSM rows:", len(osm_ml))
print("Columns:")
print(osm_ml.columns.tolist())

OSM rows: 173935
Columns:
['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry']


In [ ]:
print("Crime columns:")
print(osm_crime_features.columns.tolist())

print("\nEnvironment columns:")
print(osm_environment_features.columns.tolist())

print("\nInfrastructure columns:")
print(infra_features_osm.columns.tolist())

Crime columns:
['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry', 'historical_crime_count', 'historical_high_count', 'historical_medium_count', 'historical_low_count', 'historical_critical_count', 'crime_count_7d', 'high_severity_count_7d', 'medium_severity_count_7d', 'low_severity_count_7d', 'critical_severity_count_7d', 'crime_count_30d', 'high_severity_count_30d', 'medium_severity_count_30d', 'low_severity_count_30d', 'critical_severity_count_30d', 'crime_count_90d', 'high_severity_count_90d', 'medium_severity_count_90d', 'low_severity_count_90d', 'critical_severity_count_90d', 'historical_severity_score', 'crime_90d_severity_score', 'crime_risk', 'crime_risk_100', 'crime_risk_level']

Environment columns:
['osm_segment_id', 'geometry', 'environment_risk_100', 'environment_match_m']

Infrastructure columns:
['osm_segment_id', 'geometry', 'police_distance_km', 'hospital_distance_km', 'me

In [ ]:
# Keep only feature columns that are not geometry/duplicate identifiers
crime_cols = [
    c for c in osm_crime_features.columns
    if c not in ["geometry", "u", "v", "key"]
]

env_cols = [
    c for c in osm_environment_features.columns
    if c not in ["geometry", "u", "v", "key"]
]

infra_cols = [
    c for c in infra_features_osm.columns
    if c not in ["geometry", "u", "v", "key"]
]

print("Crime feature columns:", crime_cols)
print("Environment feature columns:", env_cols)
print("Infrastructure feature columns:", infra_cols)

Crime feature columns: ['osm_segment_id', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'historical_crime_count', 'historical_high_count', 'historical_medium_count', 'historical_low_count', 'historical_critical_count', 'crime_count_7d', 'high_severity_count_7d', 'medium_severity_count_7d', 'low_severity_count_7d', 'critical_severity_count_7d', 'crime_count_30d', 'high_severity_count_30d', 'medium_severity_count_30d', 'low_severity_count_30d', 'critical_severity_count_30d', 'crime_count_90d', 'high_severity_count_90d', 'medium_severity_count_90d', 'low_severity_count_90d', 'critical_severity_count_90d', 'historical_severity_score', 'crime_90d_severity_score', 'crime_risk', 'crime_risk_100', 'crime_risk_level']
Environment feature columns: ['osm_segment_id', 'environment_risk_100', 'environment_match_m']
Infrastructure feature columns: ['osm_segment_id', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_dis

In [ ]:
# Recreate the environment → OSM mapping

from sklearn.neighbors import BallTree
import numpy as np

# Make sure both datasets have coordinates
env_points = environment_df.copy()

# If environment_df has latitude/longitude
print(environment_df.columns.tolist())

['segment_id', 'lighting_level', 'lighting_score', 'road_condition', 'road_condition_score', 'visibility_level', 'visibility_score', 'sidewalk_available', 'sidewalk_score', 'pedestrian_density', 'pedestrian_score', 'crowd_level', 'crowd_score', 'shops_open', 'isolation_level', 'isolation_score', 'road_work_present', 'construction_level', 'environment_risk_100']


In [ ]:
from pathlib import Path

print("Cache files containing environment:")
for f in CACHE_DIR.rglob("*"):
    if f.is_file() and "env" in f.name.lower():
        print(f.name, "→", f)

Cache files containing environment:
osm_environment_features.pkl → /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/osm_environment_features.pkl


In [ ]:
print("Relevant variables currently available:")

for name in [
    "env_to_osm",
    "environment_mapping",
    "environment_osm_mapping",
    "osm_environment_mapping"
]:
    print(name, "→", name in globals())

Relevant variables currently available:
env_to_osm → False
environment_mapping → False
environment_osm_mapping → False
osm_environment_mapping → False


In [ ]:
print(osm_environment_features.columns.tolist())

['osm_segment_id', 'geometry', 'environment_risk_100', 'environment_match_m']


In [ ]:
osm_ml = osm_segments_gdf[
    ["osm_segment_id", "u", "v", "key", "length", "geometry"]
].copy()

# --- Crime Features ---
# The training data uses generic 'high_severity_count', etc.
# We map them from historical counts available in osm_crime_features.
crime_features_map = {
    "crime_count_7d": "crime_count_7d",
    "crime_count_30d": "crime_count_30d",
    "crime_count_90d": "crime_count_90d",
    "historical_high_count": "high_severity_count",
    "historical_medium_count": "medium_severity_count",
    "historical_low_count": "low_severity_count",
    "crime_risk_100": "weighted_crime_score", # Use the final crime risk score
}

# Select the necessary columns from osm_crime_features and rename them for merging
crime_data_to_merge = osm_crime_features[
    list(crime_features_map.keys()) + ["osm_segment_id"]
].copy()
crime_data_to_merge = crime_data_to_merge.rename(columns=crime_features_map)

osm_ml = osm_ml.merge(
    crime_data_to_merge,
    on="osm_segment_id",
    how="left"
)

# --- Environment Features ---
# The training data uses individual environment scores. We need to merge them
# from the original `environment_df` using the `env_to_osm` mapping.

env_raw_scores_cols = [
    "segment_id",
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score",
]

env_raw_data = environment_df[env_raw_scores_cols].copy()

# Join env_raw_data with env_to_osm to get the osm_segment_id mapping
# Ensure unique osm_segment_id mapping for merging
env_mapped_scores = env_to_osm[
    ["osm_segment_id", "segment_id"]
].drop_duplicates("osm_segment_id").merge(
    env_raw_data,
    on="segment_id",
    how="left"
).drop(columns="segment_id")

osm_ml = osm_ml.merge(
    env_mapped_scores,
    on="osm_segment_id",
    how="left"
)

# --- Infrastructure Features ---
# These are already correctly defined and merged.
# infra_cols excludes 'geometry', 'u', 'v', 'key' already
infra_cols_to_merge = [c for c in infra_cols if c != "osm_segment_id"] + ["osm_segment_id"]
osm_ml = osm_ml.merge(
    infra_features_osm[infra_cols_to_merge],
    on="osm_segment_id",
    how="left"
)

print("Result shape:", osm_ml.shape)
print("Unique segments:", osm_ml["osm_segment_id"].nunique())


Result shape: (173935, 26)
Unique segments: 173935


In [ ]:
print("Result shape:", osm_ml.shape)
print("Unique segments:", osm_ml["osm_segment_id"].nunique())
print(osm_ml.columns.tolist())

Result shape: (173935, 26)
Unique segments: 173935
['osm_segment_id', 'u', 'v', 'key', 'length', 'geometry', 'crime_count_7d', 'crime_count_30d', 'crime_count_90d', 'high_severity_count', 'medium_severity_count', 'low_severity_count', 'weighted_crime_score', 'lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'police_points_500m', 'cctv_count_500m']


In [ ]:
departure_time = pd.Timestamp("2026-09-19 20:00:00")

print("Departure time:", departure_time)

Departure time: 2026-09-19 20:00:00


In [ ]:
hour = departure_time.hour
day_of_week = departure_time.dayofweek

osm_ml["hour"] = hour
osm_ml["day_of_week"] = day_of_week
osm_ml["is_weekend"] = int(day_of_week >= 5)
osm_ml["is_night"] = int(hour < 6 or hour >= 19)

osm_ml["hour_sin"] = np.sin(
    2 * np.pi * hour / 24
)

osm_ml["hour_cos"] = np.cos(
    2 * np.pi * hour / 24
)

print(
    osm_ml[
        [
            "hour",
            "day_of_week",
            "is_weekend",
            "is_night",
            "hour_sin",
            "hour_cos"
        ]
    ].head(1)
)

   hour  day_of_week  is_weekend  is_night  hour_sin  hour_cos
0    20            5           1         1 -0.866025       0.5


In [ ]:
dynamic_defaults = {
    "traffic_speed_kmph": 30.0,
    "free_flow_speed_kmph": 40.0,
    "congestion_ratio": 0.25,
    "travel_time_min": 1.0,

    "temperature_c": 28.0,
    "rainfall_mm": 0.0,
    "humidity": 75.0,
    "wind_speed_kmh": 12.0,
    "cloud_cover": 40.0,
    "visibility_km": 8.0,
}

for col, value in dynamic_defaults.items():
    osm_ml[col] = value

print("Dynamic context added.")

Dynamic context added.


In [ ]:
print("CRIME:")
print(osm_crime_features.columns.tolist())

print("\nENVIRONMENT:")
print(osm_environment_features.columns.tolist())

CRIME:
['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry', 'historical_crime_count', 'historical_high_count', 'historical_medium_count', 'historical_low_count', 'historical_critical_count', 'crime_count_7d', 'high_severity_count_7d', 'medium_severity_count_7d', 'low_severity_count_7d', 'critical_severity_count_7d', 'crime_count_30d', 'high_severity_count_30d', 'medium_severity_count_30d', 'low_severity_count_30d', 'critical_severity_count_30d', 'crime_count_90d', 'high_severity_count_90d', 'medium_severity_count_90d', 'low_severity_count_90d', 'critical_severity_count_90d', 'historical_severity_score', 'crime_90d_severity_score', 'crime_risk', 'crime_risk_100', 'crime_risk_level']

ENVIRONMENT:
['osm_segment_id', 'geometry', 'environment_risk_100', 'environment_match_m']


In [ ]:
missing = [
    col for col in ML_FEATURES
    if col not in osm_ml.columns
]

print("Missing ML features:", missing)

if missing:
    raise ValueError(
        f"Missing required ML features: {missing}"
    )

X_osm = osm_ml[ML_FEATURES].copy()

print("Inference matrix:", X_osm.shape)

Missing ML features: []
Inference matrix: (173935, 36)


In [ ]:
print("osm_crime_features shape:", osm_crime_features.shape)

print("\nActual crime columns:")
for i, col in enumerate(osm_crime_features.columns):
    print(i, repr(col))

osm_crime_features shape: (173935, 40)

Actual crime columns:
0 'osm_segment_id'
1 'u'
2 'v'
3 'key'
4 'osmid'
5 'name'
6 'highway'
7 'oneway'
8 'length'
9 'lanes'
10 'maxspeed'
11 'bridge'
12 'tunnel'
13 'junction'
14 'geometry'
15 'historical_crime_count'
16 'historical_high_count'
17 'historical_medium_count'
18 'historical_low_count'
19 'historical_critical_count'
20 'crime_count_7d'
21 'high_severity_count_7d'
22 'medium_severity_count_7d'
23 'low_severity_count_7d'
24 'critical_severity_count_7d'
25 'crime_count_30d'
26 'high_severity_count_30d'
27 'medium_severity_count_30d'
28 'low_severity_count_30d'
29 'critical_severity_count_30d'
30 'crime_count_90d'
31 'high_severity_count_90d'
32 'medium_severity_count_90d'
33 'low_severity_count_90d'
34 'critical_severity_count_90d'
35 'historical_severity_score'
36 'crime_90d_severity_score'
37 'crime_risk'
38 'crime_risk_100'
39 'crime_risk_level'


In [ ]:
print("\nEnvironment columns:")
for i, col in enumerate(osm_environment_features.columns):
    print(i, repr(col))


Environment columns:
0 'osm_segment_id'
1 'geometry'
2 'environment_risk_100'
3 'environment_match_m'


In [ ]:
# ============================================================
# BUILD OSM INFERENCE DATASET
# ============================================================

osm_ml = osm_segments_gdf[
    ["osm_segment_id", "u", "v", "key", "length", "geometry"]
].copy()

# ============================================================
# 1. CRIME FEATURES
# ============================================================

crime_data = osm_crime_features[
    [
        "osm_segment_id",
        "crime_count_7d",
        "crime_count_30d",
        "crime_count_90d",
        "historical_high_count",
        "historical_medium_count",
        "historical_low_count",
        "historical_critical_count",
    ]
].copy()

# Recreate weighted historical crime score
crime_data["weighted_crime_score"] = (
    crime_data["historical_critical_count"] * 1.00
    + crime_data["historical_high_count"] * 0.80
    + crime_data["historical_medium_count"] * 0.50
    + crime_data["historical_low_count"] * 0.25
)

# Rename historical severity counts
crime_data = crime_data.rename(
    columns={
        "historical_high_count": "high_severity_count",
        "historical_medium_count": "medium_severity_count",
        "historical_low_count": "low_severity_count",
    }
)

osm_ml = osm_ml.merge(
    crime_data,
    on="osm_segment_id",
    how="left"
)

print("Crime features merged.")

Crime features merged.


In [ ]:
print("Shape:", osm_ml.shape)
print("Unique segments:", osm_ml["osm_segment_id"].nunique())

print(
    osm_ml[
        [
            "crime_count_7d",
            "crime_count_30d",
            "crime_count_90d",
            "high_severity_count",
            "medium_severity_count",
            "low_severity_count",
            "weighted_crime_score",
        ]
    ].isna().sum()
)

Shape: (173935, 30)
Unique segments: 173935
crime_count_7d           0
crime_count_30d          0
crime_count_90d          0
high_severity_count      0
medium_severity_count    0
low_severity_count       0
weighted_crime_score     0
dtype: int64


In [ ]:
env_raw_scores_cols = [
    "segment_id",
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score",
]

env_raw_data = environment_df[
    env_raw_scores_cols
].copy()

env_mapped_scores = (
    env_to_osm[
        ["osm_segment_id", "segment_id"]
    ]
    .drop_duplicates("osm_segment_id")
    .merge(
        env_raw_data,
        on="segment_id",
        how="left"
    )
    .drop(columns="segment_id")
)

osm_ml = osm_ml.merge(
    env_mapped_scores,
    on="osm_segment_id",
    how="left"
)

print("Environment features merged.")

Environment features merged.


In [ ]:
# ============================================================
# 2. ENVIRONMENT FEATURES
# ============================================================

env_raw_scores_cols = [
    "segment_id",
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score",
]

env_raw_data = environment_df[env_raw_scores_cols].copy()

env_mapped_scores = (
    env_to_osm[
        ["osm_segment_id", "segment_id"]
    ]
    .drop_duplicates("osm_segment_id")
    .merge(
        env_raw_data,
        on="segment_id",
        how="left"
    )
    .drop(columns="segment_id")
)

osm_ml = osm_ml.merge(
    env_mapped_scores,
    on="osm_segment_id",
    how="left"
)

print("Environment features merged.")
print("Shape:", osm_ml.shape)

Environment features merged.
Shape: (173935, 37)


In [ ]:
infra_features = [
    "police_distance_km",
    "hospital_distance_km",
    "metro_distance_km",
    "bus_stop_distance_km",
    "police_points_500m",
    "cctv_count_500m",
]

infra_data = infra_features_osm[
    ["osm_segment_id"] + infra_features
].copy()

osm_ml = osm_ml.merge(
    infra_data,
    on="osm_segment_id",
    how="left"
)

print("Infrastructure features merged.")

Infrastructure features merged.


In [ ]:
# ============================================================
# 3. INFRASTRUCTURE FEATURES
# ============================================================

infra_cols_to_merge = [
    c for c in infra_cols
    if c != "osm_segment_id"
] + ["osm_segment_id"]

osm_ml = osm_ml.merge(
    infra_features_osm[infra_cols_to_merge],
    on="osm_segment_id",
    how="left"
)

print("Infrastructure features merged.")
print("Shape:", osm_ml.shape)

Infrastructure features merged.
Shape: (173935, 43)


In [ ]:
print("OSM inference shape:", osm_ml.shape)

print(
    "Unique OSM segments:",
    osm_ml["osm_segment_id"].nunique()
)

missing = [
    c for c in ML_FEATURES
    if c not in osm_ml.columns
]

print("\nMissing ML features:")
print(missing)

print("\nAvailable ML features:",
      len([c for c in ML_FEATURES if c in osm_ml.columns]))

OSM inference shape: (173935, 30)
Unique OSM segments: 173935

Missing ML features:
['lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'police_points_500m', 'cctv_count_500m']

Available ML features: 23


In [ ]:
departure_time = pd.Timestamp("2026-09-19 20:00:00")

print("Departure:", departure_time)

Departure: 2026-09-19 20:00:00


In [ ]:
hour = departure_time.hour
day_of_week = departure_time.dayofweek

osm_ml["hour"] = hour
osm_ml["day_of_week"] = day_of_week
osm_ml["is_weekend"] = int(day_of_week >= 5)
osm_ml["is_night"] = int(hour < 6 or hour >= 19)

osm_ml["hour_sin"] = np.sin(
    2 * np.pi * hour / 24
)

osm_ml["hour_cos"] = np.cos(
    2 * np.pi * hour / 24
)

print(
    osm_ml[
        [
            "hour",
            "day_of_week",
            "is_weekend",
            "is_night",
            "hour_sin",
            "hour_cos"
        ]
    ].head(1)
)

   hour  day_of_week  is_weekend  is_night  hour_sin  hour_cos
0    20            5           1         1 -0.866025       0.5


In [ ]:
scenario = {
    # Traffic
    "traffic_speed_kmph": 30.0,
    "free_flow_speed_kmph": 40.0,
    "congestion_ratio": 0.25,
    "travel_time_min": 1.0,

    # Weather
    "temperature_c": 28.0,
    "rainfall_mm": 0.0,
    "humidity": 75.0,
    "wind_speed_kmh": 12.0,
    "cloud_cover": 40.0,
    "visibility_km": 8.0,
}

print("Inference scenario:")
for key, value in scenario.items():
    print(f"{key}: {value}")

Inference scenario:
traffic_speed_kmph: 30.0
free_flow_speed_kmph: 40.0
congestion_ratio: 0.25
travel_time_min: 1.0
temperature_c: 28.0
rainfall_mm: 0.0
humidity: 75.0
wind_speed_kmh: 12.0
cloud_cover: 40.0
visibility_km: 8.0


In [ ]:
for feature, value in scenario.items():
    osm_ml[feature] = value

In [ ]:
missing = [
    c for c in ML_FEATURES
    if c not in osm_ml.columns
]

print("Missing ML features:", missing)

print(
    "Available ML features:",
    len([c for c in ML_FEATURES if c in osm_ml.columns])
)

if missing:
    raise ValueError(
        f"Still missing ML features: {missing}"
    )

Missing ML features: []
Available ML features: 36


In [ ]:
X_osm = osm_ml[ML_FEATURES].copy()

print("Inference matrix:", X_osm.shape)

print("\nMissing values:")
print(
    X_osm.isna()
    .sum()
    .loc[lambda x: x > 0]
)

Inference matrix: (173935, 36)

Missing values:
lighting_score          173288
road_condition_score    173288
visibility_score        173288
sidewalk_score          173288
pedestrian_score        173288
crowd_score             173288
isolation_score         173288
dtype: int64


In [ ]:
X_osm = X_osm.replace(
    [np.inf, -np.inf],
    np.nan
)

training_medians = training[
    ML_FEATURES
].median()

X_osm = X_osm.fillna(training_medians)

remaining_missing = X_osm.isna().sum().sum()

print(
    "Remaining missing values:",
    remaining_missing
)

Remaining missing values: 0


In [ ]:
osm_ml["ml_safety_score"] = lgb_model.predict(X_osm)

osm_ml["ml_safety_score"] = (
    osm_ml["ml_safety_score"]
    .clip(0, 100)
)

print(
    osm_ml["ml_safety_score"].describe()
)

count    173935.000000
mean         64.650172
std           2.127921
min          33.119582
25%          63.399819
50%          64.796558
75%          65.889299
max          75.916531
Name: ml_safety_score, dtype: float64


In [ ]:
print(
    osm_ml[
        [
            "osm_segment_id",
            "ml_safety_score"
        ]
    ].head(10)
)

          osm_segment_id  ml_safety_score
0  30037235_2197652486_0        63.142962
1   30037235_254497449_0        63.174000
2   30037236_304918752_0        62.983688
3   30037236_254497666_0        62.960229
4   30037236_254491154_0        63.240990
5   30037239_304918740_0        62.489356
6   30037239_369875180_0        62.844739
7    30037239_30037236_0        63.111961
8   30037241_304918729_0        63.118718
9   30037241_254491130_0        63.352786


In [ ]:
ML_ROAD_CACHE = CACHE_DIR / "osm_ml_predictions.pkl"

osm_ml.to_pickle(ML_ROAD_CACHE)

print("Saved:", ML_ROAD_CACHE)
print(
    "Size:",
    round(
        ML_ROAD_CACHE.stat().st_size / (1024 * 1024),
        2
    ),
    "MB"
)

Saved: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/osm_ml_predictions.pkl
Size: 69.61 MB


# **Stage 3 — Hybrid Risk Layer**

In [ ]:
ML_ROAD_CACHE = CACHE_DIR / "osm_ml_predictions.pkl"

osm_ml = pd.read_pickle(ML_ROAD_CACHE)

print("Loaded:", osm_ml.shape)
print(
    "ML safety range:",
    osm_ml["ml_safety_score"].min(),
    "→",
    osm_ml["ml_safety_score"].max()
)

Loaded: (173935, 44)
ML safety range: 33.11958244866183 → 75.916531388064


In [ ]:
osm_ml["ml_risk_100"] = (
    100 - osm_ml["ml_safety_score"]
).clip(0, 100)

print(
    osm_ml["ml_risk_100"].describe()
)

count    173935.000000
mean         35.349828
std           2.127921
min          24.083469
25%          34.110701
50%          35.203442
75%          36.600181
max          66.880418
Name: ml_risk_100, dtype: float64


In [ ]:
risk_cols = [
    "osm_segment_id",
    "crime_risk_100",
]

crime_risk = osm_crime_features[
    risk_cols
].copy()

osm_ml = osm_ml.merge(
    crime_risk,
    on="osm_segment_id",
    how="left"
)

In [ ]:
env_risk = osm_environment_features[
    [
        "osm_segment_id",
        "environment_risk_100"
    ]
].copy()

osm_ml = osm_ml.merge(
    env_risk,
    on="osm_segment_id",
    how="left"
)

In [ ]:
print(infra_features_osm.columns.tolist())

['osm_segment_id', 'geometry', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'police_points_500m', 'cctv_count_500m']


In [ ]:
print("Infrastructure cache shape:", infra_features_osm.shape)

print("\nInfrastructure columns:")
for i, col in enumerate(infra_features_osm.columns):
    print(i, repr(col))

Infrastructure cache shape: (173935, 8)

Infrastructure columns:
0 'osm_segment_id'
1 'geometry'
2 'police_distance_km'
3 'hospital_distance_km'
4 'metro_distance_km'
5 'bus_stop_distance_km'
6 'police_points_500m'
7 'cctv_count_500m'


In [ ]:
# ============================================================
# VECTORISED INFRASTRUCTURE RISK
# ============================================================

infra = infra_features_osm.copy()

# ------------------------------------------------------------
# Normalize each infrastructure feature to [0, 1]
# ------------------------------------------------------------

def minmax_risk(series, higher_is_risk=True):
    x = series.astype(float).fillna(series.median())

    lo = x.min()
    hi = x.max()

    if hi == lo:
        result = np.zeros(len(x))
    else:
        result = (x - lo) / (hi - lo)

    if not higher_is_risk:
        result = 1.0 - result

    return result


# Greater distance = higher risk
police_distance_risk = minmax_risk(
    infra["police_distance_km"],
    higher_is_risk=True
)

hospital_distance_risk = minmax_risk(
    infra["hospital_distance_km"],
    higher_is_risk=True
)

metro_distance_risk = minmax_risk(
    infra["metro_distance_km"],
    higher_is_risk=True
)

bus_distance_risk = minmax_risk(
    infra["bus_stop_distance_km"],
    higher_is_risk=True
)

# Fewer safety resources = higher risk
police_point_risk = minmax_risk(
    infra["police_points_500m"],
    higher_is_risk=False
)

cctv_risk = minmax_risk(
    infra["cctv_count_500m"],
    higher_is_risk=False
)

# ------------------------------------------------------------
# Infrastructure risk
# ------------------------------------------------------------

infra["infrastructure_risk_100"] = (
    100
    * (
        police_distance_risk
        + hospital_distance_risk
        + metro_distance_risk
        + bus_distance_risk
        + police_point_risk
        + cctv_risk
    )
    / 6.0
)

infra["infrastructure_risk_100"] = (
    infra["infrastructure_risk_100"]
    .clip(0, 100)
)

print(
    infra[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ].head()
)

print(
    "\nInfrastructure risk statistics:"
)

print(
    infra["infrastructure_risk_100"].describe()
)

          osm_segment_id  infrastructure_risk_100
0  30037235_2197652486_0                59.200385
1   30037235_254497449_0                58.915978
2   30037236_304918752_0                58.853877
3   30037236_254497666_0                58.606564
4   30037236_254491154_0                56.856336

Infrastructure risk statistics:
count    173935.000000
mean         51.899811
std           7.917046
min          24.287770
25%          46.582908
50%          50.507939
75%          56.002541
max          97.054221
Name: infrastructure_risk_100, dtype: float64


In [ ]:
osm_ml = osm_ml.merge(
    infra[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ],
    on="osm_segment_id",
    how="left"
)

print("Infrastructure risk merged.")

print(
    osm_ml[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ].head()
)

Infrastructure risk merged.
          osm_segment_id  infrastructure_risk_100
0  30037235_2197652486_0                59.200385
1   30037235_254497449_0                58.915978
2   30037236_304918752_0                58.853877
3   30037236_254497666_0                58.606564
4   30037236_254491154_0                56.856336


In [ ]:
risk_columns = [
    "ml_risk_100",
    "crime_risk_100",
    "environment_risk_100",
    "infrastructure_risk_100",
]

print(
    "Available risk columns:"
)

print(
    [
        c for c in risk_columns
        if c in osm_ml.columns
    ]
)

print(
    "\nMissing:"
)

print(
    [
        c for c in risk_columns
        if c not in osm_ml.columns
    ]
)

Available risk columns:
['ml_risk_100', 'crime_risk_100', 'environment_risk_100', 'infrastructure_risk_100']

Missing:
[]


In [ ]:
risk_columns = [
    "ml_risk_100",
    "crime_risk_100",
    "environment_risk_100",
    "infrastructure_risk_100",
]

print(
    osm_ml[risk_columns]
    .isna()
    .sum()
)

ml_risk_100                     0
crime_risk_100                  0
environment_risk_100       173295
infrastructure_risk_100         0
dtype: int64


In [ ]:
for col in risk_columns:
    median_value = osm_ml[col].median()

    osm_ml[col] = osm_ml[col].fillna(median_value)

    print(
        f"{col}: filled missing values with {median_value:.3f}"
    )

ml_risk_100: filled missing values with 35.204
crime_risk_100: filled missing values with 0.000
environment_risk_100: filled missing values with 48.181
infrastructure_risk_100: filled missing values with 50.507


In [ ]:
RISK_WEIGHTS = {
    "ml_risk_100": 0.70,
    "crime_risk_100": 0.10,
    "environment_risk_100": 0.10,
    "infrastructure_risk_100": 0.10,
}

osm_ml["hybrid_risk_100"] = (
    osm_ml["ml_risk_100"] * 0.70
    + osm_ml["crime_risk_100"] * 0.10
    + osm_ml["environment_risk_100"] * 0.10
    + osm_ml["infrastructure_risk_100"] * 0.10
)

osm_ml["hybrid_risk_100"] = (
    osm_ml["hybrid_risk_100"]
    .clip(0, 100)
)

osm_ml["hybrid_safety_score"] = (
    100 - osm_ml["hybrid_risk_100"]
).clip(0, 100)

print(
    osm_ml[
        [
            "ml_risk_100",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100",
            "hybrid_risk_100",
            "hybrid_safety_score",
        ]
    ].describe()
)

         ml_risk_100  crime_risk_100  environment_risk_100  \
count  173954.000000   173954.000000         173954.000000   
mean       35.350708        0.205124             48.182952   
std         2.132276        2.652117              0.754731   
min        24.083469        0.000000             11.633333   
25%        34.110701        0.000000             48.180853   
50%        35.203595        0.000000             48.180853   
75%        36.601243        0.000000             48.180853   
max        66.880418      100.000000             86.700000   

       infrastructure_risk_100  hybrid_risk_100  hybrid_safety_score  
count            173954.000000    173954.000000        173954.000000  
mean                 51.898774        34.774180            65.225820  
std                   7.917507         2.208760             2.208760  
min                  24.287770        22.003974            32.662372  
25%                  46.582318        33.395942            63.971669  
50%            

In [ ]:
def risk_level(score):
    if score < 20:
        return "Very Low"
    elif score < 40:
        return "Low"
    elif score < 60:
        return "Moderate"
    elif score < 80:
        return "High"
    else:
        return "Very High"


osm_ml["risk_level"] = (
    osm_ml["hybrid_risk_100"]
    .apply(risk_level)
)

print(
    osm_ml["risk_level"]
    .value_counts()
    .sort_index()
)

risk_level
High            13
Low         170880
Moderate      3061
Name: count, dtype: int64


In [ ]:
HYBRID_CACHE = CACHE_DIR / "osm_hybrid_risk.pkl"

osm_ml.to_pickle(HYBRID_CACHE)

print("Saved:", HYBRID_CACHE)
print("Rows:", len(osm_ml))

Saved: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/osm_hybrid_risk.pkl
Rows: 173954


In [ ]:
[c for c in osm_ml.columns if "infrastructure" in c.lower()]

['infrastructure_risk_100_x', 'infrastructure_risk_100_y']

In [ ]:
# ============================================================
# RESET osm_ml CLEANLY
# Do NOT recompute any expensive spatial features.
# We only rebuild the dataframe from cached results.
# ============================================================

# Start from the original OSM segment master
osm_ml = osm_segments_gdf[
    [
        "osm_segment_id",
        "u",
        "v",
        "key",
        "length",
        "geometry",
    ]
].copy()

# ------------------------------------------------------------
# 1. Crime features
# ------------------------------------------------------------

crime_data = osm_crime_features[
    [
        "osm_segment_id",
        "crime_count_7d",
        "crime_count_30d",
        "crime_count_90d",
        "historical_high_count",
        "historical_medium_count",
        "historical_low_count",
        "historical_critical_count",
    ]
].copy()

crime_data["weighted_crime_score"] = (
    crime_data["historical_critical_count"] * 1.00
    + crime_data["historical_high_count"] * 0.80
    + crime_data["historical_medium_count"] * 0.50
    + crime_data["historical_low_count"] * 0.25
)

crime_data = crime_data.rename(
    columns={
        "historical_high_count": "high_severity_count",
        "historical_medium_count": "medium_severity_count",
        "historical_low_count": "low_severity_count",
    }
)

crime_data = crime_data.drop_duplicates(
    "osm_segment_id"
)

osm_ml = osm_ml.merge(
    crime_data,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

# ------------------------------------------------------------
# 2. Environment features
# ------------------------------------------------------------

env_raw = environment_df[
    [
        "segment_id",
        "lighting_score",
        "road_condition_score",
        "visibility_score",
        "sidewalk_score",
        "pedestrian_score",
        "crowd_score",
        "isolation_score",
    ]
].copy()

env_mapped = (
    env_to_osm[
        ["osm_segment_id", "segment_id"]
    ]
    .drop_duplicates("osm_segment_id")
    .merge(
        env_raw,
        on="segment_id",
        how="left"
    )
    .drop(columns="segment_id")
)

env_mapped = env_mapped.drop_duplicates(
    "osm_segment_id"
)

osm_ml = osm_ml.merge(
    env_mapped,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

# ------------------------------------------------------------
# 3. Infrastructure raw features
# ------------------------------------------------------------

infra_raw = infra_features_osm[
    [
        "osm_segment_id",
        "police_distance_km",
        "hospital_distance_km",
        "metro_distance_km",
        "bus_stop_distance_km",
        "police_points_500m",
        "cctv_count_500m",
    ]
].copy()

infra_raw = infra_raw.drop_duplicates(
    "osm_segment_id"
)

osm_ml = osm_ml.merge(
    infra_raw,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

# ------------------------------------------------------------
# 4. Infrastructure risk
# ------------------------------------------------------------

infra_risk = infra[
    [
        "osm_segment_id",
        "infrastructure_risk_100",
    ]
].copy()

infra_risk = infra_risk.drop_duplicates(
    "osm_segment_id"
)

osm_ml = osm_ml.merge(
    infra_risk,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

# ------------------------------------------------------------
# FINAL CHECK
# ------------------------------------------------------------

print("OSM inference shape:", osm_ml.shape)

print(
    "Unique segment IDs:",
    osm_ml["osm_segment_id"].nunique()
)

print(
    "Duplicate segment IDs:",
    osm_ml["osm_segment_id"].duplicated().sum()
)

print("\nML feature availability:")

missing = [
    c for c in ML_FEATURES
    if c not in osm_ml.columns
]

print("Missing:", missing)

print(
    "Available:",
    len([
        c for c in ML_FEATURES
        if c in osm_ml.columns
    ])
)

OSM inference shape: (173935, 28)
Unique segment IDs: 173935
Duplicate segment IDs: 0

ML feature availability:
Missing: ['traffic_speed_kmph', 'free_flow_speed_kmph', 'congestion_ratio', 'travel_time_min', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover', 'visibility_km', 'hour', 'day_of_week', 'is_weekend', 'is_night', 'hour_sin', 'hour_cos']
Available: 20


In [ ]:
# Remove any previous infrastructure-risk versions
infra_risk_cols = [
    c for c in osm_ml.columns
    if c.lower().startswith("infrastructure_risk_100")
]

print("Existing infrastructure risk columns:", infra_risk_cols)

osm_ml = osm_ml.drop(
    columns=infra_risk_cols,
    errors="ignore"
)

# Use the already-computed `infra` dataframe
infra_risk = infra[
    [
        "osm_segment_id",
        "infrastructure_risk_100"
    ]
].copy()

# Make absolutely sure one row exists per OSM segment
infra_risk = infra_risk.drop_duplicates(
    "osm_segment_id"
)

osm_ml = osm_ml.merge(
    infra_risk,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

print("Infrastructure risk merged successfully.")
print(
    "Column exists:",
    "infrastructure_risk_100" in osm_ml.columns
)

print(
    osm_ml[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ].head()
)

Existing infrastructure risk columns: ['infrastructure_risk_100']
Infrastructure risk merged successfully.
Column exists: True
          osm_segment_id  infrastructure_risk_100
0  30037235_2197652486_0                59.200385
1   30037235_254497449_0                58.915978
2   30037236_304918752_0                58.853877
3   30037236_254497666_0                58.606564
4   30037236_254491154_0                56.856336


In [ ]:
infra_risk = infra[
    [
        "osm_segment_id",
        "infrastructure_risk_100"
    ]
].copy()

osm_ml = osm_ml.merge(
    infra_risk,
    on="osm_segment_id",
    how="left"
)

print("Infrastructure risk merged successfully.")

print(
    osm_ml[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ].head()
)

Infrastructure risk merged successfully.


KeyError: "['infrastructure_risk_100'] not in index"

In [ ]:
# Remove all previous infrastructure risk versions
old_infra_cols = [
    c for c in osm_ml.columns
    if c.startswith("infrastructure_risk_100")
]

print("Removing:", old_infra_cols)

osm_ml = osm_ml.drop(
    columns=old_infra_cols,
    errors="ignore"
)

print(
    "Remaining infrastructure columns:",
    [
        c for c in osm_ml.columns
        if "infrastructure_risk" in c
    ]
)

Removing: ['infrastructure_risk_100_x', 'infrastructure_risk_100_y']
Remaining infrastructure columns: []


In [ ]:
infra_risk = infra[
    [
        "osm_segment_id",
        "infrastructure_risk_100"
    ]
].copy()

# Make sure there is exactly one risk value per segment
infra_risk = infra_risk.drop_duplicates(
    subset="osm_segment_id",
    keep="first"
)

print("Infrastructure risk rows:", len(infra_risk))
print(
    "Unique IDs:",
    infra_risk["osm_segment_id"].nunique()
)

Infrastructure risk rows: 173935
Unique IDs: 173935


In [ ]:
osm_ml = osm_ml.merge(
    infra_risk,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

print("Infrastructure risk merged successfully.")

print(
    "Column exists:",
    "infrastructure_risk_100" in osm_ml.columns
)

print(
    osm_ml[
        [
            "osm_segment_id",
            "infrastructure_risk_100"
        ]
    ].head()
)

Infrastructure risk merged successfully.
Column exists: True
          osm_segment_id  infrastructure_risk_100
0  30037235_2197652486_0                59.200385
1   30037235_254497449_0                58.915978
2   30037236_304918752_0                58.853877
3   30037236_254497666_0                58.606564
4   30037236_254491154_0                56.856336


In [ ]:
[c for c in osm_ml.columns if "infrastructure_risk" in c]

['infrastructure_risk_100']

In [ ]:
departure_time = pd.Timestamp("2026-09-19 20:00:00")

osm_ml["hour"] = departure_time.hour
osm_ml["day_of_week"] = departure_time.dayofweek
osm_ml["is_weekend"] = int(departure_time.dayofweek >= 5)
osm_ml["is_night"] = int(departure_time.hour < 6 or departure_time.hour >= 18)

osm_ml["hour_sin"] = np.sin(2 * np.pi * departure_time.hour / 24)
osm_ml["hour_cos"] = np.cos(2 * np.pi * departure_time.hour / 24)

print("Time features added.")

Time features added.


In [ ]:
osm_ml["traffic_speed_kmph"] = 30.0
osm_ml["free_flow_speed_kmph"] = 40.0
osm_ml["congestion_ratio"] = 0.25
osm_ml["travel_time_min"] = 1.0

osm_ml["temperature_c"] = 28.0
osm_ml["rainfall_mm"] = 0.0
osm_ml["humidity"] = 75.0
osm_ml["wind_speed_kmh"] = 12.0
osm_ml["cloud_cover"] = 40.0
osm_ml["visibility_km"] = 8.0

print("Dynamic traffic and weather features added.")

Dynamic traffic and weather features added.


In [ ]:
missing_features = [f for f in ML_FEATURES if f not in osm_ml.columns]

print("Total ML features:", len(ML_FEATURES))
print("Missing features:", missing_features)

Total ML features: 36
Missing features: []


In [ ]:
print(osm_ml[ML_FEATURES].shape)

(173935, 36)


In [ ]:
X_osm = osm_ml[ML_FEATURES].copy()

X_osm = X_osm.replace([np.inf, -np.inf], np.nan)

# Use training medians for any missing values
for col in ML_FEATURES:
    if X_osm[col].isna().any():
        X_osm[col] = X_osm[col].fillna(X_train[col].median())

print("Inference matrix:", X_osm.shape)
print("Remaining missing:", X_osm.isna().sum().sum())

Inference matrix: (173935, 36)
Remaining missing: 0


In [ ]:
osm_ml["ml_safety_score"] = lgb_model.predict(X_osm)

osm_ml["ml_safety_score"] = (
    osm_ml["ml_safety_score"]
    .clip(0, 100)
)

osm_ml["ml_risk_100"] = 100 - osm_ml["ml_safety_score"]

print(
    osm_ml[
        ["osm_segment_id", "ml_safety_score", "ml_risk_100"]
    ].head()
)

print("\nML safety statistics:")
print(osm_ml["ml_safety_score"].describe())

          osm_segment_id  ml_safety_score  ml_risk_100
0  30037235_2197652486_0        63.142962    36.857038
1   30037235_254497449_0        63.174000    36.826000
2   30037236_304918752_0        62.983688    37.016312
3   30037236_254497666_0        62.960229    37.039771
4   30037236_254491154_0        63.240990    36.759010

ML safety statistics:
count    173935.000000
mean         64.650172
std           2.127921
min          33.119582
25%          63.399819
50%          64.796558
75%          65.889299
max          75.916531
Name: ml_safety_score, dtype: float64


In [ ]:
# Make sure environment features have one row per OSM segment
env_risk = osm_environment_features[
    ["osm_segment_id", "environment_risk_100"]
].copy()

env_risk = env_risk.drop_duplicates(
    subset="osm_segment_id",
    keep="first"
)

# Merge by segment ID instead of relying on row position
osm_ml = osm_ml.drop(
    columns=["environment_risk_100"],
    errors="ignore"
)

osm_ml = osm_ml.merge(
    env_risk,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

print("Environment risk merged.")
print("OSM ML shape:", osm_ml.shape)
print(
    "Missing environment risk:",
    osm_ml["environment_risk_100"].isna().sum()
)

Environment risk merged.
OSM ML shape: (173935, 48)
Missing environment risk: 173295


In [ ]:
# Crime risk: also merge by segment ID for consistency
crime_risk = osm_crime_features[
    ["osm_segment_id", "crime_risk_100"]
].copy()

crime_risk = crime_risk.drop_duplicates(
    subset="osm_segment_id",
    keep="first"
)

osm_ml = osm_ml.drop(
    columns=["crime_risk_100"],
    errors="ignore"
)

osm_ml = osm_ml.merge(
    crime_risk,
    on="osm_segment_id",
    how="left",
    validate="one_to_one"
)

print("Crime + environment risk merged successfully.")
print(
    osm_ml[
        [
            "osm_segment_id",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100"
        ]
    ].head()
)

Crime + environment risk merged successfully.
          osm_segment_id  crime_risk_100  environment_risk_100  \
0  30037235_2197652486_0             0.0                   NaN   
1   30037235_254497449_0             0.0                   NaN   
2   30037236_304918752_0             0.0                   NaN   
3   30037236_254497666_0             0.0                   NaN   
4   30037236_254491154_0             0.0                   NaN   

   infrastructure_risk_100  
0                59.200385  
1                58.915978  
2                58.853877  
3                58.606564  
4                56.856336  


In [ ]:
osm_ml["hybrid_risk_100"] = (
    0.70 * osm_ml["ml_risk_100"] +
    0.10 * osm_ml["crime_risk_100"] +
    0.10 * osm_ml["environment_risk_100"] +
    0.10 * osm_ml["infrastructure_risk_100"]
)

osm_ml["hybrid_risk_100"] = (
    osm_ml["hybrid_risk_100"]
    .clip(0, 100)
)

osm_ml["hybrid_safety_score"] = (
    100 - osm_ml["hybrid_risk_100"]
)

print(
    osm_ml[
        [
            "osm_segment_id",
            "ml_safety_score",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100",
            "hybrid_risk_100",
            "hybrid_safety_score"
        ]
    ].head()
)

          osm_segment_id  ml_safety_score  crime_risk_100  \
0  30037235_2197652486_0        63.142962             0.0   
1   30037235_254497449_0        63.174000             0.0   
2   30037236_304918752_0        62.983688             0.0   
3   30037236_254497666_0        62.960229             0.0   
4   30037236_254491154_0        63.240990             0.0   

   environment_risk_100  infrastructure_risk_100  hybrid_risk_100  \
0                   NaN                59.200385              NaN   
1                   NaN                58.915978              NaN   
2                   NaN                58.853877              NaN   
3                   NaN                58.606564              NaN   
4                   NaN                56.856336              NaN   

   hybrid_safety_score  
0                  NaN  
1                  NaN  
2                  NaN  
3                  NaN  
4                  NaN  


In [ ]:
print("Total OSM segments:", len(osm_ml))

print(
    "Missing environment risk:",
    osm_ml["environment_risk_100"].isna().sum()
)

print(
    "Missing percentage:",
    osm_ml["environment_risk_100"].isna().mean() * 100
)

Total OSM segments: 173935
Missing environment risk: 173295
Missing percentage: 99.63204645413516


In [ ]:
print(
    "Environment rows:",
    len(osm_environment_features)
)

print(
    "Unique environment segment IDs:",
    osm_environment_features["osm_segment_id"].nunique()
)

Environment rows: 173954
Unique environment segment IDs: 173935


In [ ]:
missing_env = osm_ml[
    osm_ml["environment_risk_100"].isna()
][["osm_segment_id"]].copy()

print("Unmatched OSM segments:", len(missing_env))
print(missing_env.head(20))

Unmatched OSM segments: 173295
            osm_segment_id
0    30037235_2197652486_0
1     30037235_254497449_0
2     30037236_304918752_0
3     30037236_254497666_0
4     30037236_254491154_0
5     30037239_304918740_0
6     30037239_369875180_0
7      30037239_30037236_0
8     30037241_304918729_0
9     30037241_254491130_0
10   30037241_5460627725_0
11   30037242_6259787233_0
12     30037242_30037241_0
13    30037243_309316811_0
14    30037243_384486242_0
15  30037244_13001229874_0
16    30037247_249074525_0
17   30037247_9593473426_0
18    30037248_309316816_0
19  30037248_12655856331_0


In [ ]:
env_median = osm_ml["environment_risk_100"].median()

print("Environment risk median:", env_median)

osm_ml["environment_risk_100"] = (
    osm_ml["environment_risk_100"]
    .fillna(env_median)
)

print(
    "Remaining missing environment risk:",
    osm_ml["environment_risk_100"].isna().sum()
)

Environment risk median: 48.18319360461655
Remaining missing environment risk: 0


In [ ]:
osm_ml["hybrid_risk_100"] = (
    0.70 * osm_ml["ml_risk_100"] +
    0.10 * osm_ml["crime_risk_100"] +
    0.10 * osm_ml["environment_risk_100"] +
    0.10 * osm_ml["infrastructure_risk_100"]
)

osm_ml["hybrid_risk_100"] = (
    osm_ml["hybrid_risk_100"]
    .clip(0, 100)
)

osm_ml["hybrid_safety_score"] = (
    100 - osm_ml["hybrid_risk_100"]
)

In [ ]:
print(
    osm_ml[
        [
            "osm_segment_id",
            "ml_safety_score",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100",
            "hybrid_risk_100",
            "hybrid_safety_score"
        ]
    ].head()
)

          osm_segment_id  ml_safety_score  crime_risk_100  \
0  30037235_2197652486_0        63.142962             0.0   
1   30037235_254497449_0        63.174000             0.0   
2   30037236_304918752_0        62.983688             0.0   
3   30037236_254497666_0        62.960229             0.0   
4   30037236_254491154_0        63.240990             0.0   

   environment_risk_100  infrastructure_risk_100  hybrid_risk_100  \
0             48.183194                59.200385        36.538285   
1             48.183194                58.915978        36.488117   
2             48.183194                58.853877        36.615125   
3             48.183194                58.606564        36.606815   
4             48.183194                56.856336        36.235260   

   hybrid_safety_score  
0            63.461715  
1            63.511883  
2            63.384875  
3            63.393185  
4            63.764740  


In [ ]:
segment_risk = osm_ml[
    [
        "osm_segment_id",
        "length",
        "hybrid_risk_100",
        "hybrid_safety_score"
    ]
].copy()

segment_risk = segment_risk.drop_duplicates(
    "osm_segment_id"
)

print("Segment risk table:", segment_risk.shape)

Segment risk table: (173935, 4)


In [ ]:
risk_lookup = segment_risk.set_index(
    "osm_segment_id"
).to_dict("index")

print("Risk lookup created:", len(risk_lookup))

Risk lookup created: 173935


In [ ]:
def score_route(graph, route):
    records = get_route_edge_records(graph, route)

    total_length = 0.0
    weighted_risk = 0.0
    matched_edges = 0

    for edge in records:
        segment_id = f"{edge['u']}_{edge['v']}_{edge['key']}"

        if segment_id not in risk_lookup:
            continue

        data = risk_lookup[segment_id]

        length = float(data["length"])
        risk = float(data["hybrid_risk_100"])

        total_length += length
        weighted_risk += risk * length
        matched_edges += 1

    if total_length == 0:
        return None

    route_risk = weighted_risk / total_length
    safety_score = 100 - route_risk

    return {
        "distance_km": total_length / 1000,
        "route_risk": route_risk,
        "safety_score": safety_score,
        "matched_edges": matched_edges,
        "total_edges": len(records)
    }

In [ ]:
G = ox.graph_from_place(
    "Chennai, Tamil Nadu, India",
    network_type="drive",
    simplify=True
)

In [ ]:
[name for name in ["G", "G_chennai", "graph", "G_drive"] if name in globals()]

['G']

In [ ]:
def get_route_edge_records(graph, route):
    records = []

    for u, v in zip(route[:-1], route[1:]):
        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        # Select the edge with the shortest length
        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        records.append({
            "u": u,
            "v": v,
            "key": key
        })

    return records

print("get_route_edge_records() defined.")

get_route_edge_records() defined.


In [ ]:
def score_route(graph, route):

    records = get_route_edge_records(graph, route)

    total_length = 0.0
    weighted_risk = 0.0
    matched_edges = 0

    for edge in records:

        segment_id = (
            f"{edge['u']}_{edge['v']}_{edge['key']}"
        )

        if segment_id not in risk_lookup:
            continue

        data = risk_lookup[segment_id]

        length = float(data["length"])
        risk = float(data["hybrid_risk_100"])

        total_length += length
        weighted_risk += risk * length

        matched_edges += 1

    if total_length == 0:
        return None

    route_risk = weighted_risk / total_length
    safety_score = 100 - route_risk

    return {
        "distance_km": total_length / 1000,
        "route_risk": route_risk,
        "safety_score": safety_score,
        "matched_edges": matched_edges,
        "total_edges": len(records)
    }

print("score_route() defined.")

score_route() defined.


In [ ]:
print("Routes:", len(candidate_routes))
print("Graph nodes:", len(G.nodes))
print("Graph edges:", len(G.edges))
print("Risk lookup:", len(risk_lookup))

Routes: 20
Graph nodes: 68665
Graph edges: 173929
Risk lookup: 173935


In [ ]:
route_results = []

for i, route in enumerate(candidate_routes, start=1):

    result = score_route(G, route)

    if result is None:
        continue

    result["route_id"] = i
    result["node_count"] = len(route)

    route_results.append(result)

route_scores = pd.DataFrame(route_results)

route_scores = route_scores.sort_values(
    "safety_score",
    ascending=False
).reset_index(drop=True)

print(route_scores)

TypeError: 'float' object is not subscriptable

In [ ]:
route_scores["coverage"] = (
    route_scores["matched_edges"] /
    route_scores["total_edges"]
)

print(
    route_scores[
        [
            "route_id",
            "distance_km",
            "route_risk",
            "safety_score",
            "coverage"
        ]
    ]
)

    route_id  distance_km  route_risk  safety_score  coverage
0         17     5.570281   37.601056     62.398944       1.0
1          7     5.552697   37.610082     62.389918       1.0
2          4     5.492644   37.618204     62.381796       1.0
3          6     5.523744   37.625872     62.374128       1.0
4          3     5.468182   37.627191     62.372809       1.0
5          5     5.499282   37.634843     62.365157       1.0
6          1     5.390545   37.645039     62.354961       1.0
7          2     5.421645   37.652698     62.347302       1.0
8         18     5.571743   37.840429     62.159571       1.0
9         10     5.564761   37.843622     62.156378       1.0
10        20     5.571968   37.845198     62.154802       1.0
11         8     5.558704   37.851538     62.148462       1.0
12         9     5.560767   37.851591     62.148409       1.0
13        13     5.567383   37.852816     62.147184       1.0
14        16     5.569446   37.852868     62.147132       1.0
15      

In [ ]:
def route_edge_set(graph, route):
    records = get_route_edge_records(graph, route)

    return {
        f"{r['u']}_{r['v']}_{r['key']}"
        for r in records
    }


# Create edge sets for every candidate route
route_edge_sets = {}

for i, route in enumerate(candidate_routes, start=1):
    route_edge_sets[i] = route_edge_set(G, route)


def jaccard_similarity(set_a, set_b):
    if not set_a and not set_b:
        return 1.0

    return len(set_a & set_b) / len(set_a | set_b)

In [ ]:
selected_routes = []

for _, row in route_scores.iterrows():

    route_id = int(row["route_id"])

    is_diverse = True

    for selected_id in selected_routes:
        similarity = jaccard_similarity(
            route_edge_sets[route_id],
            route_edge_sets[selected_id]
        )

        if similarity >= 0.70:
            is_diverse = False
            break

    if is_diverse:
        selected_routes.append(route_id)

    if len(selected_routes) == 5:
        break


print("Selected route IDs:", selected_routes)

Selected route IDs: [17, 18, 19]


In [ ]:
top_routes = route_scores[
    route_scores["route_id"].isin(selected_routes)
].copy()

top_routes = top_routes.sort_values(
    "safety_score",
    ascending=False
).reset_index(drop=True)

top_routes["rank"] = range(1, len(top_routes) + 1)

top_routes = top_routes[
    [
        "rank",
        "route_id",
        "distance_km",
        "route_risk",
        "safety_score",
        "coverage"
    ]
]

print(top_routes.to_string(index=False))

 rank  route_id  distance_km  route_risk  safety_score  coverage
    1        17     5.570281   37.601056     62.398944       1.0
    2        18     5.571743   37.840429     62.159571       1.0
    3        19     5.571863   37.863167     62.136833       1.0


In [ ]:
route_details = []

for _, row in top_routes.iterrows():

    route_id = int(row["route_id"])

    route = candidate_routes[route_id - 1]

    records = get_route_edge_records(G, route)

    route_details.append({
        "route_id": route_id,
        "rank": int(row["rank"]),
        "distance_km": row["distance_km"],
        "route_risk": row["route_risk"],
        "safety_score": row["safety_score"],
        "node_count": len(route),
        "edge_count": len(records),
        "route_nodes": route
    })

route_details_df = pd.DataFrame(route_details)

print(
    route_details_df[
        [
            "rank",
            "route_id",
            "distance_km",
            "route_risk",
            "safety_score",
            "node_count",
            "edge_count"
        ]
    ].to_string(index=False)
)

 rank  route_id  distance_km  route_risk  safety_score  node_count  edge_count
    1        17     5.570281   37.601056     62.398944          41          40
    2        18     5.571743   37.840429     62.159571          90          89
    3        19     5.571863   37.863167     62.136833          96          95


In [ ]:
def get_route_road_names(graph, route):

    roads = []

    for u, v in zip(route[:-1], route[1:]):

        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        name = data.get("name")

        if isinstance(name, list):
            name = ", ".join(map(str, name))

        if not name:
            name = "Unnamed road"

        roads.append({
            "u": u,
            "v": v,
            "key": key,
            "road_name": name,
            "length_m": data.get("length", 0)
        })

    return roads

In [ ]:
for _, row in top_routes.iterrows():

    route_id = int(row["route_id"])
    route = candidate_routes[route_id - 1]

    roads = get_route_road_names(G, route)

    print(f"\n===== ROUTE {route_id} =====")

    for road in roads[:15]:
        print(
            f"{road['road_name']} "
            f"({road['length_m']:.0f} m)"
        )



===== ROUTE 17 =====
Raja Muthiah Road (60 m)
Muthu Gramani Street (14 m)
Varasidhi Vinayakar Koil Street (56 m)
Unnamed road (45 m)
Unnamed road (41 m)
Unnamed road (40 m)
Varasidhi Vinayakar Koil Street (37 m)
Varasidhi Vinayakar Koil Street (43 m)
Varasidhi Vinayakar Koil Street (40 m)
Varasidhi Vinayakar Koil Street (22 m)
EVR Periyar Salai (84 m)
General Hospital Road (8 m)
General Hospital Road (38 m)
General Hospital Road (217 m)
General Hospital Road (80 m)

===== ROUTE 18 =====
Unnamed road (28 m)
Varasidhi Vinayakar Koil Street (48 m)
Varasidhi Vinayakar Koil Street (37 m)
Varasidhi Vinayakar Koil Street (43 m)
Varasidhi Vinayakar Koil Street (40 m)
Varasidhi Vinayakar Koil Street (22 m)
EVR Periyar Salai (84 m)
General Hospital Road (8 m)
Raja Muthiah Road (11 m)
EVR Periyar Salai (9 m)
EVR Periyar Salai (620 m)
Langs Garden Road, Gandhi Irwin Bridge, Gandhi Irwin Bridge Road (225 m)
Gandhi Irwin Bridge Road (6 m)
Gandhi Irwin Bridge Road (232 m)
Gandhi Irwin Bridge Road (1

In [ ]:
def build_route_segments(graph, route, route_id, risk_lookup):

    segments = []

    for idx, (u, v) in enumerate(zip(route[:-1], route[1:]), start=1):

        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        segment_id = f"{u}_{v}_{key}"

        risk_data = risk_lookup.get(segment_id, {})

        road_name = data.get("name", "Unnamed road")

        if isinstance(road_name, list):
            road_name = ", ".join(map(str, road_name))

        if not road_name:
            road_name = "Unnamed road"

        segments.append({
            "route_id": route_id,
            "segment_order": idx,
            "osm_segment_id": segment_id,
            "u": u,
            "v": v,
            "key": key,
            "road_name": road_name,
            "length_m": float(data.get("length", 0)),
            "hybrid_risk": risk_data.get("hybrid_risk_100"),
            "safety_score": risk_data.get("hybrid_safety_score"),
        })

    return pd.DataFrame(segments)

In [ ]:
all_route_segments = []

for _, row in top_routes.iterrows():

    route_id = int(row["route_id"])

    route = candidate_routes[route_id - 1]

    segments = build_route_segments(
        G,
        route,
        route_id,
        risk_lookup
    )

    all_route_segments.append(segments)

route_segments_df = pd.concat(
    all_route_segments,
    ignore_index=True
)

print("Total route segments:", len(route_segments_df))

print(
    route_segments_df[
        [
            "route_id",
            "segment_order",
            "road_name",
            "length_m",
            "hybrid_risk",
            "safety_score"
        ]
    ].head(20)
)

Total route segments: 224
    route_id  segment_order                        road_name    length_m  \
0         17              1                Raja Muthiah Road   60.089343   
1         17              2             Muthu Gramani Street   14.021937   
2         17              3  Varasidhi Vinayakar Koil Street   56.034304   
3         17              4                     Unnamed road   44.619042   
4         17              5                     Unnamed road   41.298192   
5         17              6                     Unnamed road   39.931953   
6         17              7  Varasidhi Vinayakar Koil Street   36.512680   
7         17              8  Varasidhi Vinayakar Koil Street   42.923521   
8         17              9  Varasidhi Vinayakar Koil Street   40.129575   
9         17             10  Varasidhi Vinayakar Koil Street   22.273810   
10        17             11                EVR Periyar Salai   83.803093   
11        17             12            General Hospital Road  

In [ ]:
def calculate_bearing(lat1, lon1, lat2, lon2):

    lat1 = np.radians(lat1)
    lat2 = np.radians(lat2)

    dlon = np.radians(lon2 - lon1)

    x = np.sin(dlon) * np.cos(lat2)

    y = (
        np.cos(lat1) * np.sin(lat2)
        -
        np.sin(lat1) * np.cos(lat2) * np.cos(dlon)
    )

    bearing = np.degrees(
        np.arctan2(x, y)
    )

    return (bearing + 360) % 360

In [ ]:
def classify_turn(previous_bearing, current_bearing):

    angle = (
        current_bearing -
        previous_bearing +
        540
    ) % 360 - 180

    if abs(angle) < 25:
        return "Continue straight"

    elif 25 <= angle < 150:
        return "Turn right"

    elif -150 < angle <= -25:
        return "Turn left"

    else:
        return "Make a U-turn"

In [ ]:
def generate_turn_instructions(graph, route):

    instructions = []

    previous_bearing = None
    previous_road = None
    accumulated_distance = 0.0

    for u, v in zip(route[:-1], route[1:]):

        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        length = float(data.get("length", 0))

        road_name = data.get(
            "name",
            "Unnamed road"
        )

        if isinstance(road_name, list):
            road_name = ", ".join(
                map(str, road_name)
            )

        if not road_name:
            road_name = "Unnamed road"

        node_u = graph.nodes[u]
        node_v = graph.nodes[v]

        bearing = calculate_bearing(
            node_u["y"],
            node_u["x"],
            node_v["y"],
            node_v["x"]
        )

        # First segment
        if previous_bearing is None:

            instructions.append({
                "instruction": f"Start on {road_name}",
                "distance_m": length
            })

            previous_bearing = bearing
            previous_road = road_name
            accumulated_distance = length

            continue

        # Same road → accumulate distance
        if road_name == previous_road:

            accumulated_distance += length

        else:

            turn = classify_turn(
                previous_bearing,
                bearing
            )

            instructions.append({
                "instruction": (
                    f"{turn} onto {road_name}"
                ),
                "distance_m": length
            })

            accumulated_distance = length
            previous_road = road_name

        previous_bearing = bearing

    instructions.append({
        "instruction": "Arrive at destination",
        "distance_m": 0
    })

    return instructions

In [ ]:
route_17 = candidate_routes[17 - 1]

instructions_17 = generate_turn_instructions(
    G,
    route_17
)

for i, instruction in enumerate(
    instructions_17,
    start=1
):
    print(
        f"{i}. "
        f"{instruction['instruction']} "
        f"({instruction['distance_m']:.0f} m)"
    )

1. Start on Raja Muthiah Road (60 m)
2. Turn left onto Muthu Gramani Street (14 m)
3. Turn left onto Varasidhi Vinayakar Koil Street (56 m)
4. Turn right onto Unnamed road (45 m)
5. Turn right onto Varasidhi Vinayakar Koil Street (37 m)
6. Turn left onto EVR Periyar Salai (84 m)
7. Continue straight onto General Hospital Road (8 m)
8. Turn right onto Muthuswamy Bridge, Muthuswamy Road (447 m)
9. Turn left onto Muthuswamy Road (12 m)
10. Turn right onto Rajaji Salai (68 m)
11. Continue straight onto Kamarajar Salai, Rajaji Salai, Napier Bridge (203 m)
12. Continue straight onto Kamarajar Salai (416 m)
13. Arrive at destination (0 m)


In [ ]:
import geopandas as gpd
from shapely.geometry import LineString

route_gdfs = []

for _, row in top_routes.iterrows():

    route_id = int(row["route_id"])
    route = candidate_routes[route_id - 1]

    coordinates = [
        (G.nodes[node]["x"], G.nodes[node]["y"])
        for node in route
    ]

    line = LineString(coordinates)

    route_gdfs.append({
        "route_id": route_id,
        "rank": int(row["rank"]),
        "distance_km": row["distance_km"],
        "route_risk": row["route_risk"],
        "safety_score": row["safety_score"],
        "geometry": line
    })

routes_gdf = gpd.GeoDataFrame(
    route_gdfs,
    geometry="geometry",
    crs="EPSG:4326"
)

print(routes_gdf)

   route_id  rank  distance_km  route_risk  safety_score  \
0        17     1     5.570281   37.601056     62.398944   
1        18     2     5.571743   37.840429     62.159571   
2        19     3     5.571863   37.863167     62.136833   

                                            geometry  
0  LINESTRING (80.2707 13.08253, 80.27063 13.0830...  
1  LINESTRING (80.2707 13.08253, 80.27044 13.0825...  
2  LINESTRING (80.2707 13.08253, 80.27044 13.0825...  


In [ ]:
from shapely.geometry import Point

start_node = candidate_routes[0][0]
end_node = candidate_routes[0][-1]

start_point = Point(
    G.nodes[start_node]["x"],
    G.nodes[start_node]["y"]
)

end_point = Point(
    G.nodes[end_node]["x"],
    G.nodes[end_node]["y"]
)

print("Start:", start_point)
print("Destination:", end_point)

Start: POINT (80.2706992 13.0825329)
Destination: POINT (80.2807996 13.0500343)


In [ ]:
def risk_color(risk):

    if pd.isna(risk):
        return "gray"

    if risk < 25:
        return "green"

    elif risk < 50:
        return "yellow"

    elif risk < 75:
        return "orange"

    else:
        return "red"

In [ ]:
import folium

center_lat = (
    start_point.y + end_point.y
) / 2

center_lon = (
    start_point.x + end_point.x
) / 2

m = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=14,
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Esri"
)

# Route colors
route_colors = {
    17: "blue",
    18: "green",
    19: "purple"
}

for _, row in routes_gdf.iterrows():

    route_id = int(row["route_id"])

    coordinates = [
        [lat, lon]
        for lon, lat in row.geometry.coords
    ]

    popup_text = (
        f"<b>SafeRoute {route_id}</b><br>"
        f"Rank: {row['rank']}<br>"
        f"Distance: {row['distance_km']:.2f} km<br>"
        f"Risk: {row['route_risk']:.2f}<br>"
        f"Safety Score: {row['safety_score']:.2f}"
    )

    folium.PolyLine(
        coordinates,
        color=route_colors.get(route_id, "orange"),
        weight=6,
        opacity=0.75,
        popup=popup_text
    ).add_to(m)

# Start marker
folium.Marker(
    [start_point.y, start_point.x],
    popup="Start — Chennai Central",
    icon=folium.Icon(color="green", icon="play")
).add_to(m)

# Destination marker
folium.Marker(
    [end_point.y, end_point.x],
    popup="Destination — Marina Beach",
    icon=folium.Icon(color="red", icon="flag")
).add_to(m)

m

In [ ]:
import folium

m_risk = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=14,
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Esri"
)

for _, route_row in top_routes.iterrows():

    route_id = int(route_row["route_id"])
    route = candidate_routes[route_id - 1]

    for u, v in zip(route[:-1], route[1:]):

        edge_data = G.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        segment_id = f"{u}_{v}_{key}"

        risk_data = risk_lookup.get(
            segment_id,
            {}
        )

        risk = risk_data.get(
            "hybrid_risk_100",
            np.nan
        )

        coordinates = [
            [G.nodes[u]["y"], G.nodes[u]["x"]],
            [G.nodes[v]["y"], G.nodes[v]["x"]]
        ]

        popup = (
            f"<b>Route {route_id}</b><br>"
            f"Risk: {risk:.2f}<br>"
            f"Safety: {100-risk:.2f}"
            if not pd.isna(risk)
            else
            f"<b>Route {route_id}</b><br>"
            "Risk unavailable"
        )

        folium.PolyLine(
            coordinates,
            color=risk_color(risk),
            weight=7,
            opacity=0.9,
            popup=popup
        ).add_to(m_risk)


# Start marker
folium.Marker(
    [start_point.y, start_point.x],
    popup="Start — Chennai Central",
    icon=folium.Icon(
        color="green",
        icon="play"
    )
).add_to(m_risk)


# Destination marker
folium.Marker(
    [end_point.y, end_point.x],
    popup="Destination — Marina Beach",
    icon=folium.Icon(
        color="red",
        icon="flag"
    )
).add_to(m_risk)


m_risk

In [ ]:
legend_html = """
<div style="
    position: fixed;
    bottom: 30px;
    left: 30px;
    width: 190px;
    z-index: 9999;
    background-color: white;
    border: 2px solid grey;
    border-radius: 6px;
    padding: 10px;
    font-size: 13px;
">
<b>SafeRoute Risk</b><br><br>

<span style="color:green;">━━</span>
Low (0–25)<br>

<span style="color:#d4aa00;">━━</span>
Moderate (25–50)<br>

<span style="color:orange;">━━</span>
Elevated (50–75)<br>

<span style="color:red;">━━</span>
High (75–100)
</div>
"""

m_risk.get_root().html.add_child(
    folium.Element(legend_html)
)

m_risk

In [ ]:
print("Overall hybrid risk:")
print(osm_ml["hybrid_risk_100"].describe())

print("\nSelected route segment risk:")

selected_segment_ids = set(
    route_segments_df["osm_segment_id"]
)

selected_risks = osm_ml[
    osm_ml["osm_segment_id"].isin(selected_segment_ids)
]["hybrid_risk_100"]

print(selected_risks.describe())

Overall hybrid risk:
count    173935.000000
mean         34.773317
std           2.203539
min          22.003974
25%          33.396151
50%          34.532677
75%          36.027493
max          67.337628
Name: hybrid_risk_100, dtype: float64

Selected route segment risk:
count    145.000000
mean      37.979221
std        0.892892
min       36.217110
25%       37.485635
50%       38.130855
75%       38.487450
max       39.246851
Name: hybrid_risk_100, dtype: float64


In [ ]:
print("\nRisk percentiles:")

print(
    osm_ml["hybrid_risk_100"].quantile(
        [0, 0.10, 0.25, 0.50, 0.75, 0.90, 0.95, 0.99, 1.0]
    )
)


Risk percentiles:
0.00    22.003974
0.10    32.292837
0.25    33.396151
0.50    34.532677
0.75    36.027493
0.90    37.566174
0.95    38.886787
0.99    40.741941
1.00    67.337628
Name: hybrid_risk_100, dtype: float64


In [ ]:
import folium
import pandas as pd
import numpy as np

m_risk = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=14,
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Esri"
)

# Route identity colors
route_colors = {
    17: "blue",
    18: "green",
    19: "purple"
}


# Risk color
def risk_color(risk):

    if pd.isna(risk):
        return "gray"

    if risk < 25:
        return "#00a000"

    elif risk < 40:
        return "#d4aa00"

    elif risk < 55:
        return "#ff8c00"

    else:
        return "#d00000"


# Draw routes
for _, route_row in top_routes.iterrows():

    route_id = int(route_row["route_id"])
    route = candidate_routes[route_id - 1]

    route_color = route_colors.get(
        route_id,
        "black"
    )

    for u, v in zip(route[:-1], route[1:]):

        edge_data = G.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        segment_id = f"{u}_{v}_{key}"

        risk_data = risk_lookup.get(
            segment_id,
            {}
        )

        risk = risk_data.get(
            "hybrid_risk_100",
            np.nan
        )

        coords = [
            [G.nodes[u]["y"], G.nodes[u]["x"]],
            [G.nodes[v]["y"], G.nodes[v]["x"]]
        ]

        # Dark route-identity outline
        folium.PolyLine(
            coords,
            color=route_color,
            weight=10,
            opacity=0.45
        ).add_to(m_risk)

        # Risk-colored segment
        folium.PolyLine(
            coords,
            color=risk_color(risk),
            weight=6,
            opacity=1.0,
            popup=(
                f"<b>Route {route_id}</b><br>"
                f"Risk: {risk:.2f}<br>"
                f"Safety: {100-risk:.2f}"
            )
        ).add_to(m_risk)


# Start
folium.Marker(
    [start_point.y, start_point.x],
    popup="Start — Chennai Central",
    icon=folium.Icon(
        color="green",
        icon="play"
    )
).add_to(m_risk)


# Destination
folium.Marker(
    [end_point.y, end_point.x],
    popup="Destination — Marina Beach",
    icon=folium.Icon(
        color="red",
        icon="flag"
    )
).add_to(m_risk)


m_risk

In [ ]:
legend_html = """
<div style="
    position: fixed;
    bottom: 25px;
    left: 25px;
    width: 230px;
    z-index: 9999;
    background: white;
    border: 2px solid #555;
    border-radius: 6px;
    padding: 12px;
    font-size: 13px;
">

<b>SafeRoute Risk</b><br><br>

<span style="color:#00a000;">━━━━</span>
Low &lt; 25<br>

<span style="color:#d4aa00;">━━━━</span>
Moderate 25–40<br>

<span style="color:#ff8c00;">━━━━</span>
Elevated 40–55<br>

<span style="color:#d00000;">━━━━</span>
High &gt; 55<br>

<hr>

<b>Route identity</b><br>

<span style="color:blue;">━━━━</span>
Route 17<br>

<span style="color:green;">━━━━</span>
Route 18<br>

<span style="color:purple;">━━━━</span>
Route 19

</div>
"""

m_risk.get_root().html.add_child(
    folium.Element(legend_html)
)

m_risk

In [ ]:
risk_values = osm_ml["hybrid_risk_100"].dropna()

P25 = risk_values.quantile(0.25)
P50 = risk_values.quantile(0.50)
P75 = risk_values.quantile(0.75)

print(f"P25: {P25:.2f}")
print(f"P50: {P50:.2f}")
print(f"P75: {P75:.2f}")

P25: 33.40
P50: 34.53
P75: 36.03


In [ ]:
def risk_color(risk):

    if pd.isna(risk):
        return "gray"

    if risk < P25:
        return "#16a34a"       # green

    elif risk < P50:
        return "#eab308"       # yellow

    elif risk < P75:
        return "#f97316"       # orange

    else:
        return "#dc2626"       # red

In [ ]:
selected_route_risks = (
    route_segments_df
    .groupby("route_id")["hybrid_risk"]
    .agg(
        ["min", "mean", "max"]
    )
)

print(selected_route_risks)

               min       mean        max
route_id                                
17        36.21711  37.233075  38.964443
18        36.30548  38.113357  39.246851
19        36.30548  38.158838  39.246851


In [ ]:
for route_id in sorted(
    route_segments_df["route_id"].unique()
):

    values = route_segments_df[
        route_segments_df["route_id"] == route_id
    ]["hybrid_risk"]

    print(
        f"Route {route_id}: "
        f"min={values.min():.2f}, "
        f"mean={values.mean():.2f}, "
        f"max={values.max():.2f}"
    )

Route 17: min=36.22, mean=37.23, max=38.96
Route 18: min=36.31, mean=38.11, max=39.25
Route 19: min=36.31, mean=38.16, max=39.25


In [ ]:
m_risk = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=14,
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Esri"
)

route_colors = {
    17: "blue",
    18: "green",
    19: "purple"
}

for _, route_row in top_routes.iterrows():

    route_id = int(route_row["route_id"])
    route = candidate_routes[route_id - 1]

    for u, v in zip(route[:-1], route[1:]):

        edge_data = G.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        segment_id = f"{u}_{v}_{key}"

        risk_data = risk_lookup.get(
            segment_id,
            {}
        )

        risk = risk_data.get(
            "hybrid_risk_100",
            np.nan
        )

        coords = [
            [G.nodes[u]["y"], G.nodes[u]["x"]],
            [G.nodes[v]["y"], G.nodes[v]["x"]]
        ]

        # Risk-colored road segment
        folium.PolyLine(
            coords,
            color=risk_color(risk),
            weight=7,
            opacity=0.95,
            popup=(
                f"<b>SafeRoute {route_id}</b><br>"
                f"Risk: {risk:.2f}<br>"
                f"Safety: {100-risk:.2f}"
            )
        ).add_to(m_risk)


# Start
folium.Marker(
    [start_point.y, start_point.x],
    popup="Start — Chennai Central",
    icon=folium.Icon(
        color="green",
        icon="play"
    )
).add_to(m_risk)


# Destination
folium.Marker(
    [end_point.y, end_point.x],
    popup="Destination — Marina Beach",
    icon=folium.Icon(
        color="red",
        icon="flag"
    )
).add_to(m_risk)


m_risk

In [ ]:
legend_html = f"""
<div style="
    position: fixed;
    bottom: 25px;
    left: 25px;
    width: 250px;
    z-index: 9999;
    background: white;
    border: 2px solid #555;
    border-radius: 6px;
    padding: 12px;
    font-size: 13px;
">

<b>SafeRoute Relative Risk</b><br><br>

<span style="color:#16a34a;">━━━━</span>
Low (&lt; {P25:.1f})<br>

<span style="color:#eab308;">━━━━</span>
Moderate ({P25:.1f}–{P50:.1f})<br>

<span style="color:#f97316;">━━━━</span>
Elevated ({P50:.1f}–{P75:.1f})<br>

<span style="color:#dc2626;">━━━━</span>
High (&gt; {P75:.1f})<br>

<hr>

<b>Risk is relative to the Chennai OSM network</b>

</div>
"""

m_risk.get_root().html.add_child(
    folium.Element(legend_html)
)

m_risk

In [ ]:
from branca.colormap import LinearColormap

risk_min = osm_ml["hybrid_risk_100"].quantile(0.01)
risk_max = osm_ml["hybrid_risk_100"].quantile(0.99)

risk_colormap = LinearColormap(
    colors=[
        "green",
        "yellow",
        "orange",
        "red"
    ],
    vmin=risk_min,
    vmax=risk_max
)

risk_colormap.caption = "Hybrid Risk Score"

print("Visualization range:")
print("Min:", risk_min)
print("Max:", risk_max)

Visualization range:
Min: 30.308331344049535
Max: 40.74194144361952


In [ ]:
risk_lookup = (
    osm_ml[
        [
            "osm_segment_id",
            "hybrid_risk_100"
        ]
    ]
    .drop_duplicates("osm_segment_id")
    .set_index("osm_segment_id")["hybrid_risk_100"]
    .to_dict()
)

print("Risk lookup:", len(risk_lookup))

Risk lookup: 173935


In [ ]:
high_risk_threshold = osm_ml[
    "hybrid_risk_100"
].quantile(0.75)

print(
    "High-risk threshold:",
    high_risk_threshold
)

High-risk threshold: 36.02749315149992


In [ ]:
high_risk_segments = set(
    osm_ml[
        osm_ml["hybrid_risk_100"] >= high_risk_threshold
    ]["osm_segment_id"]
)

print(
    "High-risk segments:",
    len(high_risk_segments)
)

High-risk segments: 43485


In [ ]:
m_final = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=14,
    tiles="https://server.arcgisonline.com/ArcGIS/rest/services/World_Street_Map/MapServer/tile/{z}/{y}/{x}",
    attr="Esri"
)

# ------------------------------------------------
# BACKGROUND: HIGH-RISK CHENNAI ROAD SEGMENTS
# ------------------------------------------------

for segment_id in high_risk_segments:

    parts = segment_id.split("_")

    if len(parts) != 3:
        continue

    u = int(parts[0])
    v = int(parts[1])
    key = int(parts[2])

    if u not in G.nodes or v not in G.nodes:
        continue

    risk = risk_lookup.get(segment_id)

    if risk is None:
        continue

    coords = [
        [G.nodes[u]["y"], G.nodes[u]["x"]],
        [G.nodes[v]["y"], G.nodes[v]["x"]]
    ]

    folium.PolyLine(
        coords,
        color=risk_colormap(risk),
        weight=2,
        opacity=0.45
    ).add_to(m_final)


# ------------------------------------------------
# SELECTED ROUTES
# ------------------------------------------------

route_colors = {
    17: "blue",
    18: "purple",
    19: "cyan"
}

for _, route_row in top_routes.iterrows():

    route_id = int(route_row["route_id"])
    route = candidate_routes[route_id - 1]

    # Draw route outline
    route_color = route_colors.get(
        route_id,
        "black"
    )

    for u, v in zip(route[:-1], route[1:]):

        edge_data = G.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        segment_id = f"{u}_{v}_{key}"

        risk = risk_lookup.get(
            segment_id,
            np.nan
        )

        coords = [
            [G.nodes[u]["y"], G.nodes[u]["x"]],
            [G.nodes[v]["y"], G.nodes[v]["x"]]
        ]

        # White/dark-ish outline
        folium.PolyLine(
            coords,
            color="white",
            weight=9,
            opacity=0.9
        ).add_to(m_final)

        # Route identity
        folium.PolyLine(
            coords,
            color=route_color,
            weight=6,
            opacity=1.0,
            popup=(
                f"<b>SafeRoute {route_id}</b><br>"
                f"Risk: {risk:.2f}<br>"
                f"Safety: {100-risk:.2f}"
                if not pd.isna(risk)
                else
                f"<b>SafeRoute {route_id}</b>"
            )
        ).add_to(m_final)


# ------------------------------------------------
# START / DESTINATION
# ------------------------------------------------

folium.Marker(
    [start_point.y, start_point.x],
    popup="Start — Chennai Central",
    icon=folium.Icon(
        color="green",
        icon="play"
    )
).add_to(m_final)

folium.Marker(
    [end_point.y, end_point.x],
    popup="Destination — Marina Beach",
    icon=folium.Icon(
        color="red",
        icon="flag"
    )
).add_to(m_final)


# Add continuous risk scale
risk_colormap.add_to(m_final)

m_final

**Testing-phase:1**

In [ ]:
def select_diverse_routes(
    graph,
    candidate_routes,
    risk_lookup,
    max_routes=5,
    similarity_threshold=0.70
):
    """
    Score candidate routes and select up to max_routes
    while avoiding highly overlapping routes.
    """

    # ------------------------------------------------
    # Score all candidate routes
    # ------------------------------------------------

    route_results = []

    for route_id, route in enumerate(candidate_routes, start=1):

        result = score_route(
            graph,
            route
        )

        if result is None:
            continue

        result["route_id"] = route_id
        result["node_count"] = len(route)

        route_results.append(result)

    if not route_results:
        return pd.DataFrame(), []

    route_scores = pd.DataFrame(
        route_results
    )

    # Best safety first
    route_scores = route_scores.sort_values(
        "safety_score",
        ascending=False
    ).reset_index(drop=True)

    # ------------------------------------------------
    # Build edge sets
    # ------------------------------------------------

    route_edge_sets = {}

    for route_id, route in enumerate(
        candidate_routes,
        start=1
    ):

        route_edge_sets[route_id] = (
            route_edge_set(
                graph,
                route
            )
        )

    # ------------------------------------------------
    # Select diverse routes
    # ------------------------------------------------

    selected_routes = []

    for _, row in route_scores.iterrows():

        route_id = int(
            row["route_id"]
        )

        is_diverse = True

        for selected_id in selected_routes:

            similarity = jaccard_similarity(
                route_edge_sets[route_id],
                route_edge_sets[selected_id]
            )

            if similarity >= similarity_threshold:
                is_diverse = False
                break

        if is_diverse:

            selected_routes.append(
                route_id
            )

        if len(selected_routes) >= max_routes:
            break

    # ------------------------------------------------
    # Final result
    # ------------------------------------------------

    selected_df = route_scores[
        route_scores["route_id"].isin(
            selected_routes
        )
    ].copy()

    selected_df = selected_df.sort_values(
        "safety_score",
        ascending=False
    ).reset_index(drop=True)

    selected_df["rank"] = (
        range(1, len(selected_df) + 1)
    )

    return selected_df, selected_routes

In [ ]:
def build_route_result(
    graph,
    route,
    route_id,
    rank,
    route_score
):
    """
    Build the complete API-ready representation
    of one SafeRoute.
    """

    instructions = generate_turn_instructions(
        graph,
        route
    )

    return {
        "rank": int(rank),

        "route_id": int(route_id),

        "distance_km": round(
            float(route_score["distance_km"]),
            3
        ),

        "risk_score": round(
            float(route_score["route_risk"]),
            3
        ),

        "safety_score": round(
            float(route_score["safety_score"]),
            3
        ),

        "coverage": round(
            float(route_score["coverage"]),
            3
        ),

        "instructions": instructions,

        "route_nodes": [
            int(node)
            for node in route
        ]
    }

In [ ]:
def get_safe_routes(
    graph,
    candidate_routes,
    risk_lookup,
    max_routes=5,
    similarity_threshold=0.70
):
    """
    Main SafeRoute route-selection engine.

    Input:
        graph
        candidate_routes
        risk_lookup

    Output:
        API-ready route results.
    """

    # ------------------------------------------------
    # Select routes
    # ------------------------------------------------

    route_scores, selected_route_ids = (
        select_diverse_routes(
            graph=graph,
            candidate_routes=candidate_routes,
            risk_lookup=risk_lookup,
            max_routes=max_routes,
            similarity_threshold=similarity_threshold
        )
    )

    if route_scores.empty:
        return {
            "route_count": 0,
            "routes": []
        }

    # ------------------------------------------------
    # Build complete route objects
    # ------------------------------------------------

    routes = []

    for _, row in route_scores.iterrows():

        route_id = int(
            row["route_id"]
        )

        route = candidate_routes[
            route_id - 1
        ]

        route_result = build_route_result(
            graph=graph,
            route=route,
            route_id=route_id,
            rank=row["rank"],
            route_score=row
        )

        routes.append(
            route_result
        )

    # ------------------------------------------------
    # Final response
    # ------------------------------------------------

    return {
        "route_count": len(routes),
        "routes": routes
    }

In [ ]:
risk_lookup = {}

for _, row in osm_ml.iterrows():
    risk_lookup[row["osm_segment_id"]] = {
        "length": row["length"],
        "hybrid_risk_100": row["hybrid_risk_100"]
    }

In [ ]:
sample_key = next(iter(risk_lookup))

print(sample_key)
print(risk_lookup[sample_key])

30037235_2197652486_0
{'length': 12.498709171778236, 'hybrid_risk_100': 36.538284511449746}


In [ ]:
def score_route(graph, route, risk_lookup):
    total_length = 0.0
    weighted_risk = 0.0
    covered_segments = 0

    for u, v in zip(route[:-1], route[1:]):

        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        # Select shortest OSM edge if multiple edges exist
        key = min(
            edge_data,
            key=lambda k: edge_data[k].get("length", float("inf"))
        )

        segment_id = f"{u}_{v}_{key}"

        if segment_id not in risk_lookup:
            continue

        data = risk_lookup[segment_id]

        length = float(data["length"])
        risk = float(data["hybrid_risk_100"])

        total_length += length
        weighted_risk += risk * length
        covered_segments += 1

    if total_length == 0:
        return {
            "distance_km": 0,
            "route_risk": None,
            "safety_score": None,
            "coverage": 0
        }

    route_risk = weighted_risk / total_length
    safety_score = 100 - route_risk

    return {
        "distance_km": total_length / 1000,
        "route_risk": route_risk,
        "safety_score": safety_score,
        "coverage": covered_segments / max(len(route) - 1, 1)
    }

In [ ]:
print(type(risk_lookup))

sample_key = next(iter(risk_lookup))
print("Key:", sample_key)
print("Value:", risk_lookup[sample_key])
print("Value type:", type(risk_lookup[sample_key]))

<class 'dict'>
Key: 30037235_2197652486_0
Value: {'length': 12.498709171778236, 'hybrid_risk_100': 36.538284511449746}
Value type: <class 'dict'>


In [ ]:
saferoute_result = get_safe_routes(
    graph=G,
    candidate_routes=candidate_routes,
    risk_lookup=risk_lookup,
    max_routes=5,
    similarity_threshold=0.70
)

In [ ]:
print(
    "Routes returned:",
    saferoute_result["route_count"]
)

Routes returned: 3


In [ ]:
for route in saferoute_result["routes"]:

    print(
        f"\nRoute {route['rank']}"
    )

    print(
        f"  Route ID: {route['route_id']}"
    )

    print(
        f"  Distance: {route['distance_km']} km"
    )

    print(
        f"  Risk: {route['risk_score']}"
    )

    print(
        f"  Safety: {route['safety_score']}"
    )

    print(
        f"  Coverage: {route['coverage']}"
    )

    print(
        f"  Instructions: "
        f"{len(route['instructions'])}"
    )


Route 1
  Route ID: 17
  Distance: 5.57 km
  Risk: 37.601
  Safety: 62.399
  Coverage: 1.0
  Instructions: 13

Route 2
  Route ID: 18
  Distance: 5.572 km
  Risk: 37.84
  Safety: 62.16
  Coverage: 1.0
  Instructions: 28

Route 3
  Route ID: 19
  Distance: 5.572 km
  Risk: 37.863
  Safety: 62.137
  Coverage: 1.0
  Instructions: 21


In [ ]:
import json

print(
    json.dumps(
        saferoute_result,
        indent=2
    )[:10000]
)

{
  "route_count": 3,
  "routes": [
    {
      "rank": 1,
      "route_id": 17,
      "distance_km": 5.57,
      "risk_score": 37.601,
      "safety_score": 62.399,
      "coverage": 1.0,
      "instructions": [
        {
          "instruction": "Start on Raja Muthiah Road",
          "distance_m": 60.08934320876761
        },
        {
          "instruction": "Turn left onto Muthu Gramani Street",
          "distance_m": 14.021937418489719
        },
        {
          "instruction": "Turn left onto Varasidhi Vinayakar Koil Street",
          "distance_m": 56.03430408443263
        },
        {
          "instruction": "Turn right onto Unnamed road",
          "distance_m": 44.61904188604983
        },
        {
          "instruction": "Turn right onto Varasidhi Vinayakar Koil Street",
          "distance_m": 36.51267970514292
        },
        {
          "instruction": "Turn left onto EVR Periyar Salai",
          "distance_m": 83.80309253303734
        },
        {
          

In [ ]:
print("Number of routes:", saferoute_result["route_count"])

for route in saferoute_result["routes"]:
    print("\n" + "=" * 60)
    print("Route:", route.get("route_id"))
    print("Rank:", route.get("rank"))
    print("Distance:", route.get("distance_km"), "km")
    print("Risk:", route.get("route_risk"))
    print("Safety Score:", route.get("safety_score"))

Number of routes: 3

Route: 17
Rank: 1
Distance: 5.57 km
Risk: None
Safety Score: 62.399

Route: 18
Rank: 2
Distance: 5.572 km
Risk: None
Safety Score: 62.16

Route: 19
Rank: 3
Distance: 5.572 km
Risk: None
Safety Score: 62.137


In [ ]:
import pprint

pprint.pp(
    saferoute_result["routes"][0],
    depth=4
)

{'rank': 1,
 'route_id': 17,
 'distance_km': 5.57,
 'risk_score': 37.601,
 'safety_score': 62.399,
 'coverage': 1.0,
 'instructions': [{'instruction': 'Start on Raja Muthiah Road',
                   'distance_m': 60.08934320876761},
                  {'instruction': 'Turn left onto Muthu Gramani Street',
                   'distance_m': 14.021937418489719},
                  {'instruction': 'Turn left onto Varasidhi Vinayakar Koil '
                                  'Street',
                   'distance_m': 56.03430408443263},
                  {'instruction': 'Turn right onto Unnamed road',
                   'distance_m': 44.61904188604983},
                  {'instruction': 'Turn right onto Varasidhi Vinayakar Koil '
                                  'Street',
                   'distance_m': 36.51267970514292},
                  {'instruction': 'Turn left onto EVR Periyar Salai',
                   'distance_m': 83.80309253303734},
                  {'instruction': 'Continue stra

In [ ]:
route = saferoute_result["routes"][0]

print("Route:", route["route_id"])

for i, step in enumerate(route.get("navigation", []), 1):
    print(f"{i}. {step}")

Route: 17


In [ ]:
print(saferoute_result["routes"][0].keys())

dict_keys(['rank', 'route_id', 'distance_km', 'risk_score', 'safety_score', 'coverage', 'instructions', 'route_nodes'])


In [ ]:
for route in saferoute_result["routes"]:
    print(
        "Rank:", route["rank"],
        "| Route:", route["route_id"],
        "| Distance:", round(route["distance_km"], 3), "km",
        "| Risk:", round(route["risk_score"], 3),
        "| Safety:", round(route["safety_score"], 3),
        "| Coverage:", round(route["coverage"], 3)
    )

Rank: 1 | Route: 17 | Distance: 5.57 km | Risk: 37.601 | Safety: 62.399 | Coverage: 1.0
Rank: 2 | Route: 18 | Distance: 5.572 km | Risk: 37.84 | Safety: 62.16 | Coverage: 1.0
Rank: 3 | Route: 19 | Distance: 5.572 km | Risk: 37.863 | Safety: 62.137 | Coverage: 1.0


In [ ]:
print("Route count:", saferoute_result["route_count"])

for route in saferoute_result["routes"]:
    print(
        route["rank"],
        route["route_id"],
        route["distance_km"],
        route["risk_score"],
        route["safety_score"],
        route["coverage"],
        len(route["instructions"]),
        len(route["route_nodes"])
    )

Route count: 3
1 17 5.57 37.601 62.399 1.0 13 41
2 18 5.572 37.84 62.16 1.0 28 90
3 19 5.572 37.863 62.137 1.0 21 96


# **Real Weather Data Integration**

In [ ]:
!pip -q install requests

import requests
import pandas as pd
import numpy as np
from pathlib import Path

In [ ]:
CHENNAI_LAT = 13.0827
CHENNAI_LON = 80.2707

START_DATE = "2026-03-01"
END_DATE = "2026-08-27"

url = "https://archive-api.open-meteo.com/v1/archive"

params = {
    "latitude": CHENNAI_LAT,
    "longitude": CHENNAI_LON,
    "start_date": START_DATE,
    "end_date": END_DATE,
    "hourly": ",".join([
        "temperature_2m",
        "relative_humidity_2m",
        "precipitation",
        "wind_speed_10m",
        "cloud_cover",
        "visibility"
    ]),
    "timezone": "Asia/Kolkata"
}

response = requests.get(
    url,
    params=params,
    timeout=60
)

response.raise_for_status()

weather_json = response.json()

print("Weather data downloaded successfully")
print(weather_json.keys())

Weather data downloaded successfully
dict_keys(['latitude', 'longitude', 'generationtime_ms', 'utc_offset_seconds', 'timezone', 'timezone_abbreviation', 'elevation', 'hourly_units', 'hourly'])


In [ ]:
weather_df = pd.DataFrame(weather_json["hourly"])

weather_df["timestamp"] = pd.to_datetime(
    weather_df["time"]
)

weather_df = weather_df.drop(
    columns=["time"]
)

weather_df.head()

,temperature_2m,relative_humidity_2m,precipitation,wind_speed_10m,cloud_cover,visibility,timestamp
0,25.7,87,0.0,8.5,0,None,2026-03-01 00:00:00
1,25.3,89,0.0,7.9,0,None,2026-03-01 01:00:00
2,25.0,90,0.0,7.6,0,None,2026-03-01 02:00:00
3,24.6,92,0.0,5.2,0,None,2026-03-01 03:00:00
4,24.2,93,0.0,5.0,2,None,2026-03-01 04:00:00


In [ ]:
weather_df = weather_df.rename(columns={
    "temperature_2m": "temperature_c",
    "relative_humidity_2m": "humidity",
    "precipitation": "rainfall_mm",
    "wind_speed_10m": "wind_speed_kmh",
    "cloud_cover": "cloud_cover"
})

# Open-Meteo visibility is in meters
weather_df["visibility_km"] = (
    weather_df["visibility"] / 1000.0
)

weather_df = weather_df.drop(
    columns=["visibility"]
)

weather_df.head()

,temperature_c,humidity,rainfall_mm,wind_speed_kmh,cloud_cover,timestamp,visibility_km
0,25.7,87,0.0,8.5,0,2026-03-01 00:00:00,NaN
1,25.3,89,0.0,7.9,0,2026-03-01 01:00:00,NaN
2,25.0,90,0.0,7.6,0,2026-03-01 02:00:00,NaN
3,24.6,92,0.0,5.2,0,2026-03-01 03:00:00,NaN
4,24.2,93,0.0,5.0,2,2026-03-01 04:00:00,NaN


In [ ]:
print("Rows:", len(weather_df))
print("Start:", weather_df["timestamp"].min())
print("End:", weather_df["timestamp"].max())

print("\nMissing values:")
print(weather_df.isna().sum())

Rows: 4320
Start: 2026-03-01 00:00:00
End: 2026-08-27 23:00:00

Missing values:
temperature_c        0
humidity             0
rainfall_mm          0
wind_speed_kmh       0
cloud_cover          0
timestamp            0
visibility_km     4320
dtype: int64


In [ ]:
WEATHER_CACHE = CACHE_DIR / "chennai_real_weather_2026.csv"

weather_df.to_csv(
    WEATHER_CACHE,
    index=False
)

print("Saved:", WEATHER_CACHE)

Saved: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/chennai_real_weather_2026.csv


In [ ]:
print(
    [c for c in osm_ml.columns if "time" in c.lower()]
)

['travel_time_min']


In [ ]:
[
    (name, value.shape)
    for name, value in globals().items()
    if isinstance(value, pd.DataFrame)
    and value.shape[0] > 100000
]

[('osm_segments_gdf', (173935, 15)),
 ('osm_projected', (173935, 15)),
 ('osm_crime_features', (173935, 40)),
 ('osm_environment_features', (173954, 4)),
 ('infra_features_osm', (173935, 9)),
 ('df', (173935, 9)),
 ('static_risk', (173954, 11)),
 ('training', (279840, 49)),
 ('X', (279840, 36)),
 ('X_train', (195570, 36)),
 ('osm_ml', (173935, 44)),
 ('crime_data_to_merge', (173935, 8)),
 ('X_osm', (173935, 36)),
 ('crime_data', (173935, 9)),
 ('infra_data', (173935, 7))]

In [ ]:
training["timestamp"] = pd.to_datetime(
    training["timestamp"]
)

training = training.merge(
    weather_df,
    on="timestamp",
    how="left",
    validate="many_to_one"
)

In [ ]:
weather_df = weather_df.drop(columns=["visibility_km"])

print(weather_df.columns.tolist())

['temperature_c', 'humidity', 'rainfall_mm', 'wind_speed_kmh', 'cloud_cover', 'timestamp']


In [ ]:
for name, value in list(globals().items()):
    if isinstance(value, pd.DataFrame):
        if value.shape[0] > 100000:
            print(
                name,
                "→",
                value.shape,
                "→",
                value.columns.tolist()[:15]
            )

osm_edges → (173935, 21) → ['u', 'v', 'key', 'osmid', 'highway', 'name', 'oneway', 'reversed', 'length', 'lanes', 'ref', 'geometry', 'access', 'maxspeed', 'bridge']
osm_segments_gdf → (173935, 15) → ['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry']
osm_projected → (173935, 15) → ['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry']
osm_crime_features → (173935, 40) → ['osm_segment_id', 'u', 'v', 'key', 'osmid', 'name', 'highway', 'oneway', 'length', 'lanes', 'maxspeed', 'bridge', 'tunnel', 'junction', 'geometry']
osm_environment_features → (173954, 4) → ['osm_segment_id', 'geometry', 'environment_risk_100', 'environment_match_m']
infra_features_osm → (173935, 8) → ['osm_segment_id', 'geometry', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'police_poi

In [ ]:
for name, value in list(globals().items()):
    if isinstance(value, pd.DataFrame):
        cols = set(value.columns)

        if (
            value.shape[0] > 100000
            and "timestamp" in cols
            and "target_risk_score" in cols
            and "safety_score" in cols
        ):
            print("Training DataFrame:", name)
            print("Shape:", value.shape)
            print("Columns:", value.columns.tolist())

Training DataFrame: training
Shape: (279840, 55)
Columns: ['segment_id', 'timestamp', 'hour', 'day_of_week', 'is_weekend', 'is_night', 'hour_sin', 'hour_cos', 'crime_count_7d', 'crime_count_30d', 'crime_count_90d', 'weighted_crime_score', 'high_severity_count', 'medium_severity_count', 'low_severity_count', 'lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'shops_open', 'police_distance_km', 'hospital_distance_km', 'metro_distance_km', 'bus_stop_distance_km', 'cctv_count_500m', 'police_points_500m', 'traffic_speed_kmph', 'free_flow_speed_kmph', 'congestion_ratio', 'travel_time_min', 'temperature_c_x', 'rainfall_mm_x', 'humidity_x', 'wind_speed_kmh_x', 'cloud_cover_x', 'visibility_km_x', 'city_complaint_context_score', 'fuzzy_crime_risk', 'fuzzy_environment_risk', 'fuzzy_dynamic_risk', 'fuzzy_infrastructure_risk', 'target_risk_score', 'safety_score', 'risk_level', 'split', 'data_source', 'temperature_c_y

In [ ]:
weather_cols = [
    "temperature_c_x", "temperature_c_y",
    "rainfall_mm_x", "rainfall_mm_y",
    "humidity_x", "humidity_y",
    "wind_speed_kmh_x", "wind_speed_kmh_y",
    "cloud_cover_x", "cloud_cover_y",
    "visibility_km_x", "visibility_km_y"
]

training[weather_cols].describe()

,temperature_c_x,temperature_c_y,rainfall_mm_x,rainfall_mm_y,humidity_x,humidity_y,wind_speed_kmh_x,wind_speed_kmh_y,cloud_cover_x,cloud_cover_y,visibility_km_x
count,279840.000000,279840.000000,279840.000000,279840.00000,279840.000000,279840.000000,279840.000000,279840.000000,279840.000000,279840.000000,279840.000000
mean,28.536648,30.734091,0.047386,0.07500,72.658239,67.375000,10.089773,11.375852,41.172159,62.346591,9.955682
std,1.766819,3.121818,0.185791,0.26968,10.147106,15.503922,3.892600,4.151761,17.044275,39.271334,0.771343
min,24.200000,23.700000,0.000000,0.00000,43.700000,33.000000,2.000000,0.600000,0.000000,0.000000,7.500000
25%,27.300000,28.375000,0.000000,0.00000,64.200000,55.750000,7.300000,8.800000,29.250000,20.000000,9.475000
50%,28.500000,30.500000,0.000000,0.00000,72.700000,69.000000,10.100000,11.400000,41.750000,84.000000,9.900000
75%,29.600000,32.800000,0.000000,0.00000,80.925000,80.000000,12.850000,14.200000,52.700000,98.000000,10.500000
max,33.500000,39.200000,2.000000,2.00000,95.300000,96.000000,20.400000,23.800000,84.700000,100.000000,12.100000


In [ ]:
for col in weather_cols:
    print(
        f"{col:25} "
        f"missing={training[col].isna().sum():6} "
        f"unique={training[col].nunique():6}"
    )

temperature_c_x           missing=     0 unique=    79
temperature_c_y           missing=     0 unique=   117
rainfall_mm_x             missing=     0 unique=    35
rainfall_mm_y             missing=     0 unique=    15
humidity_x                missing=     0 unique=   228
humidity_y                missing=     0 unique=    63
wind_speed_kmh_x          missing=     0 unique=   136
wind_speed_kmh_y          missing=     0 unique=   143
cloud_cover_x             missing=     0 unique=   268
cloud_cover_y             missing=     0 unique=    80
visibility_km_x           missing=     0 unique=    39
visibility_km_y           missing=279840 unique=     0


In [ ]:
pairs = [
    ("temperature_c_x", "temperature_c_y"),
    ("rainfall_mm_x", "rainfall_mm_y"),
    ("humidity_x", "humidity_y"),
    ("wind_speed_kmh_x", "wind_speed_kmh_y"),
    ("cloud_cover_x", "cloud_cover_y"),
    ("visibility_km_x", "visibility_km_y"),
]

for x, y in pairs:
    print(
        x.replace("_x", ""),
        "→",
        (training[x].fillna(-999) == training[y].fillna(-999)).mean()
    )

temperature_c → 0.014204545454545454
rainfall_mm → 0.7443181818181818
humidity → 0.0
wind_speed_kmh → 0.008522727272727272
cloud_cover → 0.0
visibility_km → 0.0


/tmp/ipykernel_8072/3672239809.py:14: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  (training[x].fillna(-999) == training[y].fillna(-999)).mean()


In [ ]:
training["temperature_c"] = training["temperature_c_y"]
training["rainfall_mm"] = training["rainfall_mm_y"]
training["humidity"] = training["humidity_y"]
training["wind_speed_kmh"] = training["wind_speed_kmh_y"]
training["cloud_cover"] = training["cloud_cover_y"]

training.drop(
    columns=[
        "temperature_c_x", "temperature_c_y",
        "rainfall_mm_x", "rainfall_mm_y",
        "humidity_x", "humidity_y",
        "wind_speed_kmh_x", "wind_speed_kmh_y",
        "cloud_cover_x", "cloud_cover_y",
        "visibility_km_x", "visibility_km_y"
    ],
    inplace=True
)

In [ ]:
print([
    c for c in training.columns
    if any(w in c.lower() for w in ["temperature", "rainfall", "humidity", "wind", "cloud", "visibility"])
])

['visibility_score', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover']


In [ ]:
weather_training_cols = [
    c for c in training.columns
    if any(x in c.lower() for x in [
        "temperature", "rainfall", "humidity",
        "wind", "cloud", "visibility"
    ])
]

print(weather_training_cols)

['visibility_score', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover']


In [ ]:
print(
    training[
        ["timestamp", "temperature_c", "rainfall_mm",
         "humidity", "wind_speed_kmh", "cloud_cover"]
    ].head(10)
)

print(
    training[
        ["temperature_c", "rainfall_mm",
         "humidity", "wind_speed_kmh", "cloud_cover"]
    ].isna().sum()
)

            timestamp  temperature_c  rainfall_mm  humidity  wind_speed_kmh  \
0 2026-03-01 14:00:00           31.7          0.0        44            16.4   
1 2026-03-01 19:00:00           27.1          0.0        80            12.3   
2 2026-03-02 02:00:00           24.9          0.0        90             5.2   
3 2026-03-02 11:00:00           31.4          0.0        48            10.4   
4 2026-03-03 03:00:00           24.2          0.0        89             0.6   
5 2026-03-03 14:00:00           31.8          0.0        44            12.7   
6 2026-03-04 03:00:00           23.7          0.0        93             2.6   
7 2026-03-04 16:00:00           29.3          0.0        59            11.8   
8 2026-03-05 20:00:00           27.2          0.0        80            11.0   
9 2026-03-05 21:00:00           26.9          0.0        80            10.9   

   cloud_cover  
0           16  
1            1  
2            0  
3            5  
4            0  
5            0  
6          

In [ ]:
# Check the Open-Meteo weather dataframe
print(weather_df.shape)
print(weather_df.columns.tolist())
print(weather_df.head())

print(
    training[
        ["timestamp",
         "temperature_c",
         "rainfall_mm",
         "humidity",
         "wind_speed_kmh",
         "cloud_cover"]
    ].head(10)
)

print("\nMissing values:")
print(
    training[
        ["temperature_c",
         "rainfall_mm",
         "humidity",
         "wind_speed_kmh",
         "cloud_cover"]
    ].isna().sum()
)

(4320, 6)
['temperature_c', 'humidity', 'rainfall_mm', 'wind_speed_kmh', 'cloud_cover', 'timestamp']
   temperature_c  humidity  rainfall_mm  wind_speed_kmh  cloud_cover  \
0           25.7        87          0.0             8.5            0   
1           25.3        89          0.0             7.9            0   
2           25.0        90          0.0             7.6            0   
3           24.6        92          0.0             5.2            0   
4           24.2        93          0.0             5.0            2   

            timestamp  
0 2026-03-01 00:00:00  
1 2026-03-01 01:00:00  
2 2026-03-01 02:00:00  
3 2026-03-01 03:00:00  
4 2026-03-01 04:00:00  
            timestamp  temperature_c  rainfall_mm  humidity  wind_speed_kmh  \
0 2026-03-01 14:00:00           31.7          0.0        44            16.4   
1 2026-03-01 19:00:00           27.1          0.0        80            12.3   
2 2026-03-02 02:00:00           24.9          0.0        90             5.2   
3 2026

In [ ]:
check = training[
    ["timestamp",
     "temperature_c",
     "rainfall_mm",
     "humidity",
     "wind_speed_kmh",
     "cloud_cover"]
].merge(
    weather_df,
    on="timestamp",
    how="left",
    suffixes=("_training", "_openmeteo")
)

print(check.head(10))

print("\nMissing Open-Meteo matches:")
print(check["temperature_c_openmeteo"].isna().sum())

            timestamp  temperature_c_training  rainfall_mm_training  \
0 2026-03-01 14:00:00                    31.7                   0.0   
1 2026-03-01 19:00:00                    27.1                   0.0   
2 2026-03-02 02:00:00                    24.9                   0.0   
3 2026-03-02 11:00:00                    31.4                   0.0   
4 2026-03-03 03:00:00                    24.2                   0.0   
5 2026-03-03 14:00:00                    31.8                   0.0   
6 2026-03-04 03:00:00                    23.7                   0.0   
7 2026-03-04 16:00:00                    29.3                   0.0   
8 2026-03-05 20:00:00                    27.2                   0.0   
9 2026-03-05 21:00:00                    26.9                   0.0   

   humidity_training  wind_speed_kmh_training  cloud_cover_training  \
0                 44                     16.4                    16   
1                 80                     12.3                     1   
2    

In [ ]:
for col in [
    "temperature_c",
    "rainfall_mm",
    "humidity",
    "wind_speed_kmh",
    "cloud_cover"
]:
    match = (
        check[f"{col}_training"].round(6)
        == check[f"{col}_openmeteo"].round(6)
    ).mean()

    print(f"{col}: {match:.2%} match")

temperature_c: 100.00% match
rainfall_mm: 100.00% match
humidity: 100.00% match
wind_speed_kmh: 100.00% match
cloud_cover: 100.00% match


# **Retraining the LightGBM model using the real Open-Meteo weather features.**

In [ ]:
crime_features = [
    "crime_count_7d",
    "crime_count_30d",
    "crime_count_90d",
    "high_severity_count",
    "medium_severity_count",
    "low_severity_count",
    "weighted_crime_score"
]

environment_features = [
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score"
]

infrastructure_features = [
    "police_distance_km",
    "hospital_distance_km",
    "metro_distance_km",
    "bus_stop_distance_km",
    "police_points_500m",
    "cctv_count_500m"
]

traffic_features = [
    "traffic_speed_kmph",
    "free_flow_speed_kmph",
    "congestion_ratio",
    "travel_time_min"
]

weather_features = [
    "temperature_c",
    "rainfall_mm",
    "humidity",
    "wind_speed_kmh",
    "cloud_cover"
]

time_features = [
    "hour",
    "day_of_week",
    "is_weekend",
    "is_night",
    "hour_sin",
    "hour_cos"
]

ML_FEATURES = (
    crime_features
    + environment_features
    + infrastructure_features
    + traffic_features
    + weather_features
    + time_features
)

print("Total features:", len(ML_FEATURES))

Total features: 35


In [ ]:
# ============================================================
# FIX WEATHER COLUMN NAMES IN TRAINING
# ============================================================

weather_rename = {
    "temperature_c_x": "temperature_c",
    "rainfall_mm_x": "rainfall_mm",
    "humidity_x": "humidity",
    "wind_speed_kmh_x": "wind_speed_kmh",
    "cloud_cover_x": "cloud_cover",
}

training = training.rename(columns=weather_rename)

print("Weather columns restored:")
print([
    c for c in [
        "temperature_c",
        "rainfall_mm",
        "humidity",
        "wind_speed_kmh",
        "cloud_cover"
    ]
    if c in training.columns
])

Weather columns restored:
['temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover']


In [ ]:
missing_features = [
    col for col in ML_FEATURES
    if col not in training.columns
]

print("Missing:", missing_features)
print("ML feature count:", len(ML_FEATURES))

Missing: []
ML feature count: 35


In [ ]:
print(
    training[
        [
            "temperature_c",
            "rainfall_mm",
            "humidity",
            "wind_speed_kmh",
            "cloud_cover"
        ]
    ].describe()
)

       temperature_c    rainfall_mm       humidity  wind_speed_kmh  \
count  279840.000000  279840.000000  279840.000000   279840.000000   
mean       28.536648       0.047386      72.658239       10.089773   
std         1.766819       0.185791      10.147106        3.892600   
min        24.200000       0.000000      43.700000        2.000000   
25%        27.300000       0.000000      64.200000        7.300000   
50%        28.500000       0.000000      72.700000       10.100000   
75%        29.600000       0.000000      80.925000       12.850000   
max        33.500000       2.000000      95.300000       20.400000   

         cloud_cover  
count  279840.000000  
mean       41.172159  
std        17.044275  
min         0.000000  
25%        29.250000  
50%        41.750000  
75%        52.700000  
max        84.700000  


In [ ]:
print("Target:", "safety_score")
print("Target missing:", training["safety_score"].isna().sum())

print("\nSplit distribution:")
print(training["split"].value_counts())

Target: safety_score
Target missing: 0

Split distribution:
split
train         189210
validation     47700
test           42930
Name: count, dtype: int64


In [ ]:
X = training[ML_FEATURES].copy()
y = training["safety_score"].copy()

train_mask = training["split"].eq("train")
val_mask = training["split"].eq("validation")
test_mask = training["split"].eq("test")

X_train = X.loc[train_mask]
y_train = y.loc[train_mask]

X_val = X.loc[val_mask]
y_val = y.loc[val_mask]

X_test = X.loc[test_mask]
y_test = y.loc[test_mask]

print("Train:", X_train.shape, y_train.shape)
print("Validation:", X_val.shape, y_val.shape)
print("Test:", X_test.shape, y_test.shape)

Train: (189210, 35) (189210,)
Validation: (47700, 35) (47700,)
Test: (42930, 35) (42930,)


In [ ]:
import lightgbm as lgb
import numpy as np
from sklearn.metrics import mean_absolute_error, mean_squared_error, r2_score

lgb_model_real_weather = lgb.LGBMRegressor(
    objective="regression",
    n_estimators=2000,
    learning_rate=0.03,
    num_leaves=31,
    max_depth=-1,
    subsample=0.8,
    colsample_bytree=0.8,
    random_state=42,
    n_jobs=-1
)

lgb_model_real_weather.fit(
    X_train,
    y_train,
    eval_set=[(X_val, y_val)],
    callbacks=[
        lgb.early_stopping(100),
        lgb.log_evaluation(100)
    ]
)

[LightGBM] [Info] Auto-choosing row-wise multi-threading, the overhead of testing was 0.128172 seconds.
You can set `force_row_wise=true` to remove the overhead.
And if memory is not enough, you can set `force_col_wise=true`.
[LightGBM] [Info] Total Bins 4315
[LightGBM] [Info] Number of data points in the train set: 189210, number of used features: 35
[LightGBM] [Info] Start training from score 57.466187
Training until validation scores don't improve for 100 rounds
[100]	valid_0's l2: 26.923
[200]	valid_0's l2: 21.9717
[300]	valid_0's l2: 21.2049
[400]	valid_0's l2: 21.0467
[500]	valid_0's l2: 21.0087
[600]	valid_0's l2: 20.9956
[700]	valid_0's l2: 20.9831
[800]	valid_0's l2: 20.9704
[900]	valid_0's l2: 20.9618
[1000]	valid_0's l2: 20.9571
[1100]	valid_0's l2: 20.9548
Early stopping, best iteration is:
[1063]	valid_0's l2: 20.952


LGBMRegressor(colsample_bytree=0.8, learning_rate=0.03, n_estimators=2000,
              n_jobs=-1, objective='regression', random_state=42,
              subsample=0.8)

In [ ]:
def evaluate_model(model, X, y, name):
    pred = model.predict(X)

    mae = mean_absolute_error(y, pred)
    rmse = np.sqrt(mean_squared_error(y, pred))
    r2 = r2_score(y, pred)

    print(
        f"{name}: "
        f"MAE={mae:.4f} | "
        f"RMSE={rmse:.4f} | "
        f"R²={r2:.4f}"
    )

    return {
        "split": name,
        "MAE": mae,
        "RMSE": rmse,
        "R2": r2
    }

real_weather_results = []

real_weather_results.append(
    evaluate_model(
        lgb_model_real_weather,
        X_train,
        y_train,
        "Train"
    )
)

real_weather_results.append(
    evaluate_model(
        lgb_model_real_weather,
        X_val,
        y_val,
        "Validation"
    )
)

real_weather_results.append(
    evaluate_model(
        lgb_model_real_weather,
        X_test,
        y_test,
        "Test"
    )
)

Train: MAE=3.5051 | RMSE=4.3982 | R²=0.8656
Validation: MAE=3.6542 | RMSE=4.5773 | R²=0.8627
Test: MAE=3.6915 | RMSE=4.6230 | R²=0.8596


In [ ]:
# ============================================================
# BUILD OSM INFERENCE MATRIX
# ============================================================

missing = [
    col for col in ML_FEATURES
    if col not in osm_ml.columns
]

print("Missing ML features:", missing)
print("Available:", len([c for c in ML_FEATURES if c in osm_ml.columns]))

if missing:
    raise ValueError(f"Still missing ML features: {missing}")

X_osm = osm_ml[ML_FEATURES].copy()

print("X_osm shape:", X_osm.shape)
print("\nMissing values:")
print(X_osm.isna().sum().loc[lambda x: x > 0])

Missing ML features: []
Available: 35
X_osm shape: (173935, 35)

Missing values:
lighting_score          173288
road_condition_score    173288
visibility_score        173288
sidewalk_score          173288
pedestrian_score        173288
crowd_score             173288
isolation_score         173288
dtype: int64


In [ ]:
print("Environment mappings:", env_to_osm.shape)
print("Unique environment segments:", env_to_osm["segment_id"].nunique())
print("Unique OSM segments:", env_to_osm["osm_segment_id"].nunique())

print("\nEnvironment score coverage:")
print(
    env_to_osm["segment_id"].notna().sum(),
    "of",
    len(environment_df)
)

Environment mappings: (795, 6)
Unique environment segments: 795
Unique OSM segments: 647

Environment score coverage:
795 of 795


In [ ]:
print(
    osm_ml[
        [
            "lighting_score",
            "road_condition_score",
            "visibility_score",
            "sidewalk_score",
            "pedestrian_score",
            "crowd_score",
            "isolation_score",
        ]
    ].notna().sum()
)

lighting_score          647
road_condition_score    647
visibility_score        647
sidewalk_score          647
pedestrian_score        647
crowd_score             647
isolation_score         647
dtype: int64


In [ ]:
# ============================================================
# MAP ENVIRONMENT FEATURES TO ALL OSM SEGMENTS
# ============================================================

env_source = road_gdf[
    ["segment_id", "geometry"]
].merge(
    environment_df[
        [
            "segment_id",
            "lighting_score",
            "road_condition_score",
            "visibility_score",
            "sidewalk_score",
            "pedestrian_score",
            "crowd_score",
            "isolation_score",
        ]
    ],
    on="segment_id",
    how="left"
)

# Make sure both are in the projected CRS
env_source = env_source.to_crs(projected_crs)

osm_for_join = osm_segments_gdf[
    ["osm_segment_id", "geometry"]
].copy()

osm_for_join = osm_for_join.set_geometry("geometry")
osm_for_join = osm_for_join.to_crs(projected_crs)

# Nearest environment road for every OSM segment
osm_env_all = gpd.sjoin_nearest(
    osm_for_join,
    env_source,
    how="left",
    distance_col="environment_match_m"
)

# Keep nearest match when multiple matches exist
osm_env_all = (
    osm_env_all
    .sort_values("environment_match_m")
    .drop_duplicates("osm_segment_id")
)

print("OSM environment mapping:", osm_env_all.shape)
print(
    "Missing environment mappings:",
    osm_env_all["lighting_score"].isna().sum()
)

print(
    "Distance statistics (m):"
)
print(
    osm_env_all["environment_match_m"].describe()
)

OSM environment mapping: (173935, 12)
Missing environment mappings: 0
Distance statistics (m):
count    173935.000000
mean        484.850075
std         599.236319
min           0.000000
25%         134.850656
50%         293.160808
75%         609.479544
max        6401.128677
Name: environment_match_m, dtype: float64


In [ ]:
environment_feature_cols = [
    "lighting_score",
    "road_condition_score",
    "visibility_score",
    "sidewalk_score",
    "pedestrian_score",
    "crowd_score",
    "isolation_score",
]

osm_ml = osm_ml.drop(
    columns=environment_feature_cols,
    errors="ignore"
)

osm_ml = osm_ml.merge(
    osm_env_all[
        ["osm_segment_id"] + environment_feature_cols
    ],
    on="osm_segment_id",
    how="left"
)

print("Environment features updated.")
print(
    osm_ml[environment_feature_cols]
    .notna()
    .sum()
)

Environment features updated.
lighting_score          173935
road_condition_score    173935
visibility_score        173935
sidewalk_score          173935
pedestrian_score        173935
crowd_score             173935
isolation_score         173935
dtype: int64


In [ ]:
X_osm = osm_ml[ML_FEATURES].copy()

print("X_osm shape:", X_osm.shape)

print("\nMissing features:")
print(
    X_osm.isna()
    .sum()
    .loc[lambda x: x > 0]
)

X_osm shape: (173935, 35)

Missing features:
Series([], dtype: int64)


In [ ]:
# ============================================================
# INFERENCE TIMESTAMP
# ============================================================

INFERENCE_TIMESTAMP = pd.Timestamp("2026-08-27 18:00:00")

print("Inference time:", INFERENCE_TIMESTAMP)

Inference time: 2026-08-27 18:00:00


In [ ]:
# ============================================================
# REAL WEATHER FOR INFERENCE
# ============================================================

weather_row = weather_df[
    weather_df["timestamp"] == INFERENCE_TIMESTAMP
]

if weather_row.empty:
    raise ValueError(
        f"No weather data found for {INFERENCE_TIMESTAMP}"
    )

weather_row = weather_row.iloc[0]

for col in [
    "temperature_c",
    "rainfall_mm",
    "humidity",
    "wind_speed_kmh",
    "cloud_cover"
]:
    X_osm[col] = weather_row[col]

print("Weather assigned:")
print(X_osm[
    [
        "temperature_c",
        "rainfall_mm",
        "humidity",
        "wind_speed_kmh",
        "cloud_cover"
    ]
].head())

Weather assigned:
   temperature_c  rainfall_mm  humidity  wind_speed_kmh  cloud_cover
0           31.5          0.1        67             9.6           98
1           31.5          0.1        67             9.6           98
2           31.5          0.1        67             9.6           98
3           31.5          0.1        67             9.6           98
4           31.5          0.1        67             9.6           98


In [ ]:
print("X_osm shape:", X_osm.shape)
print("Feature order matches:", list(X_osm.columns) == ML_FEATURES)
print("Missing values:", X_osm.isna().sum().sum())

X_osm shape: (173935, 35)
Feature order matches: True
Missing values: 0


In [ ]:
# ============================================================
# LIGHTGBM OSM RISK PREDICTION
# ============================================================

osm_ml["ml_risk_100"] = lgb_model_real_weather.predict(X_osm)

osm_ml["ml_risk_100"] = osm_ml["ml_risk_100"].clip(0, 100)

print(osm_ml["ml_risk_100"].describe())

count    173935.000000
mean         63.524004
std           5.287453
min          34.596037
25%          59.787685
50%          63.419823
75%          67.395883
max          76.822730
Name: ml_risk_100, dtype: float64


In [ ]:
print("osm_ml columns:")
print(osm_ml.columns.tolist())

print("\ninfra_features_osm columns:")
print(infra_features_osm.columns.tolist())

osm_ml columns:
['osm_segment_id', 'u', 'v', 'key', 'length', 'geometry', 'crime_count_7d', 'crime_count_30d', 'crime_count_90d', 'high_severity_count', 'medium_severity_count', 'low_severity_count', 'historical_critical_count', 'weighted_crime_score', 'hour', 'day_of_week', 'is_weekend', 'is_night', 'hour_sin', 'hour_cos', 'traffic_speed_kmph', 'free_flow_speed_kmph', 'congestion_ratio', 'travel_time_min', 'temperature_c', 'rainfall_mm', 'humidity', 'wind_speed_kmh', 'cloud_cover', 'visibility_km', 'police_distance_km_x', 'hospital_distance_km_x', 'metro_distance_km_x', 'bus_stop_distance_km_x', 'police_points_500m_x', 'cctv_count_500m_x', 'ml_safety_score', 'lighting_score', 'road_condition_score', 'visibility_score', 'sidewalk_score', 'pedestrian_score', 'crowd_score', 'isolation_score', 'ml_risk_100', 'crime_risk_100', 'environment_risk_100', 'police_distance_km_y', 'hospital_distance_km_y', 'metro_distance_km_y', 'bus_stop_distance_km_y', 'police_points_500m_y', 'cctv_count_500m_y

In [ ]:
print("osm_ml shape:", osm_ml.shape)
print("infra_features_osm shape:", infra_features_osm.shape)

osm_ml shape: (173935, 53)
infra_features_osm shape: (173935, 9)


In [ ]:
# ============================================================
# FIX DUPLICATE INFRASTRUCTURE COLUMNS
# ============================================================

infra_raw_cols = [
    "police_distance_km",
    "hospital_distance_km",
    "metro_distance_km",
    "bus_stop_distance_km",
    "police_points_500m",
    "cctv_count_500m",
]

# Remove existing duplicated versions
osm_ml = osm_ml.drop(
    columns=[
        f"{c}_x" for c in infra_raw_cols
    ] + [
        f"{c}_y" for c in infra_raw_cols
    ],
    errors="ignore"
)

# Add the canonical infrastructure features
osm_ml = osm_ml.merge(
    infra_features_osm[
        ["osm_segment_id"] + infra_raw_cols + ["infrastructure_risk_100"]
    ],
    on="osm_segment_id",
    how="left"
)

print("Infrastructure columns restored.")

print(
    osm_ml[
        infra_raw_cols + ["infrastructure_risk_100"]
    ].isna().sum()
)

Infrastructure columns restored.
police_distance_km             0
hospital_distance_km           0
metro_distance_km              0
bus_stop_distance_km           0
police_points_500m             0
cctv_count_500m                0
infrastructure_risk_100    19892
dtype: int64


In [ ]:
missing = [
    col for col in ML_FEATURES
    if col not in osm_ml.columns
]

print("Missing ML features:", missing)
print("Available ML features:",
      len([c for c in ML_FEATURES if c in osm_ml.columns]))

print(
    "\nMissing values in ML features:",
    osm_ml[ML_FEATURES].isna().sum().sum()
)

Missing ML features: []
Available ML features: 35

Missing values in ML features: 0


In [ ]:
X_osm = osm_ml[ML_FEATURES].copy()

print("X_osm:", X_osm.shape)

X_osm: (173935, 35)


In [ ]:
# ============================================================
# RESTORE ORIGINAL OSM ENVIRONMENT RISK
# ============================================================

print(osm_environment_features.columns.tolist())

['osm_segment_id', 'geometry', 'environment_risk_100', 'environment_match_m']


In [ ]:
# ============================================================
# RESTORE ORIGINAL ENVIRONMENT RISK
# ============================================================

osm_ml = osm_ml.drop(
    columns=["environment_risk_100"],
    errors="ignore"
)

osm_ml = osm_ml.merge(
    osm_environment_features[
        ["osm_segment_id", "environment_risk_100"]
    ],
    on="osm_segment_id",
    how="left"
)

print(
    osm_ml["environment_risk_100"].describe()
)

print(
    "Missing environment risk:",
    osm_ml["environment_risk_100"].isna().sum()
)

count    659.000000
mean      48.734743
std       12.258958
min       11.633333
25%       47.620832
50%       48.180853
75%       48.321372
max       86.700000
Name: environment_risk_100, dtype: float64
Missing environment risk: 173295


In [ ]:
print(
    "Missing infrastructure risk:",
    infra_features_osm["infrastructure_risk_100"].isna().sum()
)

print(
    infra_features_osm["infrastructure_risk_100"].describe()
)

Missing infrastructure risk: 19892
count    154043.000000
mean         59.103851
std          14.941224
min          11.633333
25%          47.938857
50%          48.291335
75%          69.194763
max          86.700000
Name: infrastructure_risk_100, dtype: float64


In [ ]:
print(infra.columns.tolist())

NameError: name 'infra' is not defined

In [ ]:
# ============================================================
# FINAL HYBRID RISK
# ============================================================

osm_ml["hybrid_risk_100"] = (
    0.70 * osm_ml["ml_risk_100"]
    + 0.10 * osm_ml["crime_risk_100"]
    + 0.10 * osm_ml["environment_risk_100"]
    + 0.10 * osm_ml["infrastructure_risk_100"]
).clip(0, 100)

osm_ml["safety_score"] = (
    100 - osm_ml["hybrid_risk_100"]
).clip(0, 100)

print(
    osm_ml[
        [
            "ml_risk_100",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100",
            "hybrid_risk_100",
            "safety_score"
        ]
    ].describe()
)

         ml_risk_100  crime_risk_100  environment_risk_100  \
count  173935.000000   173935.000000         173935.000000   
mean       63.524004        0.118685             99.407905   
std         5.287453        1.144694              0.087209   
min        34.596037        0.000000             99.184633   
25%        59.787685        0.000000             99.349685   
50%        63.419823        0.000000             99.409891   
75%        67.395883        0.000000             99.476369   
max        76.822730      100.000000             99.662827   

       infrastructure_risk_100  hybrid_risk_100   safety_score  
count            154043.000000    154043.000000  154043.000000  
mean                 59.103851        60.141806      39.858194  
std                  14.941224         3.659277       3.659277  
min                  11.633333        41.892624      28.808654  
25%                  47.938857        57.367042      37.099799  
50%                  48.291335        60.139154    

In [ ]:
# ============================================================
# HYBRID RISK CALCULATION
# ============================================================

# ML risk
ml_risk = osm_ml["ml_risk_100"]

# Crime risk: normalize weighted crime score to 0–100
crime_min = osm_ml["weighted_crime_score"].min()
crime_max = osm_ml["weighted_crime_score"].max()

if crime_max > crime_min:
    osm_ml["crime_risk_100"] = (
        (osm_ml["weighted_crime_score"] - crime_min)
        / (crime_max - crime_min)
        * 100
    )
else:
    osm_ml["crime_risk_100"] = 0.0


# Environment risk
# Higher environment scores = safer conditions,
# so convert to risk.
environment_safety = osm_ml[
    [
        "lighting_score",
        "road_condition_score",
        "visibility_score",
        "sidewalk_score",
        "pedestrian_score",
        "crowd_score",
    ]
].mean(axis=1)

osm_ml["environment_risk_100"] = (
    100 - environment_safety
).clip(0, 100)


# Infrastructure risk
# Use the previously calculated infrastructure risk if available.
if "infrastructure_risk_100" not in osm_ml.columns:
    raise ValueError(
        "infrastructure_risk_100 is missing from osm_ml"
    )


# ============================================================
# HYBRID WEIGHTS
# ============================================================

osm_ml["hybrid_risk_100"] = (
    0.70 * osm_ml["ml_risk_100"]
    + 0.10 * osm_ml["crime_risk_100"]
    + 0.10 * osm_ml["environment_risk_100"]
    + 0.10 * osm_ml["infrastructure_risk_100"]
).clip(0, 100)

osm_ml["safety_score"] = (
    100 - osm_ml["hybrid_risk_100"]
).clip(0, 100)


print("Hybrid risk calculated.")

print(
    osm_ml[
        [
            "ml_risk_100",
            "crime_risk_100",
            "environment_risk_100",
            "infrastructure_risk_100",
            "hybrid_risk_100",
            "safety_score",
        ]
    ].describe()
)

Hybrid risk calculated.
         ml_risk_100  crime_risk_100  environment_risk_100  \
count  173935.000000   173935.000000         173935.000000   
mean       63.524004        0.118685             99.407905   
std         5.287453        1.144694              0.087209   
min        34.596037        0.000000             99.184633   
25%        59.787685        0.000000             99.349685   
50%        63.419823        0.000000             99.409891   
75%        67.395883        0.000000             99.476369   
max        76.822730      100.000000             99.662827   

       infrastructure_risk_100  hybrid_risk_100   safety_score  
count            154043.000000    154043.000000  154043.000000  
mean                 59.103851        60.141806      39.858194  
std                  14.941224         3.659277       3.659277  
min                  11.633333        41.892624      28.808654  
25%                  47.938857        57.367042      37.099799  
50%                  48.291

In [ ]:
MODEL_PATH_REAL_WEATHER = CACHE_DIR / "saferoute_lightgbm_real_weather.txt"

lgb_model_real_weather.booster_.save_model(
    str(MODEL_PATH_REAL_WEATHER)
)

print("Saved:", MODEL_PATH_REAL_WEATHER)

Saved: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/saferoute_lightgbm_real_weather.txt


In [ ]:
import json

FEATURES_PATH = CACHE_DIR / "saferoute_ml_features_35.json"

with open(FEATURES_PATH, "w") as f:
    json.dump(ML_FEATURES, f, indent=2)

print("Saved:", FEATURES_PATH)

Saved: /content/drive/MyDrive/chennai_safe_route_dataset/_saferoute_cache/saferoute_ml_features_35.json


# **Real Time Traffic Integration**

In [ ]:
from google.colab import userdata

TOMTOM_API_KEY = userdata.get("TOMTOM_API_KEY")

print("API key loaded:", bool(TOMTOM_API_KEY))

API key loaded: True


In [ ]:
# ============================================================
# TOMTOM TRAFFIC API — CONNECTION TEST
# ============================================================

import requests
from google.colab import userdata

TOMTOM_API_KEY = userdata.get("TOMTOM_API_KEY")

if not TOMTOM_API_KEY:
    raise ValueError("TOMTOM_API_KEY was not loaded from Colab Secrets.")

url = "https://api.tomtom.com/traffic/services/4/flowSegmentData/absolute/10/json"

params = {
    "point": "13.0827,80.2707",   # Chennai Central
    "unit": "KMPH",
    "openLr": "false",
    "key": TOMTOM_API_KEY
}

response = requests.get(
    url,
    params=params,
    timeout=20
)

print("HTTP status:", response.status_code)

if response.ok:
    traffic_data = response.json()
    print("TomTom API connection: SUCCESS")
    print(traffic_data)
else:
    print("TomTom API request failed")
    print(response.text)


HTTP status: 200
TomTom API connection: SUCCESS
{'flowSegmentData': {'frc': 'FRC2', 'currentSpeed': 23, 'freeFlowSpeed': 23, 'currentTravelTime': 406, 'freeFlowTravelTime': 406, 'confidence': 1, 'roadClosure': False, 'coordinates': {'coordinate': [{'latitude': 13.080843740241827, 'longitude': 80.27090904774866}, {'latitude': 13.080885297069777, 'longitude': 80.27090904774866}, {'latitude': 13.080925547586018, 'longitude': 80.27090636553964}, {'latitude': 13.080961715894244, 'longitude': 80.27090368333063}, {'latitude': 13.081095856999955, 'longitude': 80.27089697780809}, {'latitude': 13.08121652678199, 'longitude': 80.27088759007654}, {'latitude': 13.08126886054595, 'longitude': 80.270880884554}, {'latitude': 13.08136136310001, 'longitude': 80.27082992258266}, {'latitude': 13.081496810289993, 'longitude': 80.27078968944744}, {'latitude': 13.081824038637288, 'longitude': 80.27074006858066}, {'latitude': 13.081986346349012, 'longitude': 80.27072263422207}, {'latitude': 13.082060070591243

In [ ]:
# ============================================================
# TOMTOM TRAFFIC PARSER
# ============================================================

def parse_tomtom_traffic(response_json):
    data = response_json["flowSegmentData"]

    current_speed = float(data["currentSpeed"])
    free_flow_speed = float(data["freeFlowSpeed"])
    current_travel_time = float(data["currentTravelTime"])

    # Congestion ratio:
    # 0 = no congestion
    # higher = more congestion
    if free_flow_speed > 0:
        congestion_ratio = (
            1 - current_speed / free_flow_speed
        )
    else:
        congestion_ratio = 0.0

    congestion_ratio = max(0.0, min(1.0, congestion_ratio))

    return {
        "traffic_speed_kmph": current_speed,
        "free_flow_speed_kmph": free_flow_speed,
        "congestion_ratio": congestion_ratio,
        "travel_time_min": current_travel_time / 60.0,
        "confidence": float(data.get("confidence", 0)),
        "road_closure": bool(data.get("roadClosure", False))
    }


traffic_features = parse_tomtom_traffic(traffic_data)

print(traffic_features)

{'traffic_speed_kmph': 23.0, 'free_flow_speed_kmph': 23.0, 'congestion_ratio': 0.0, 'travel_time_min': 6.766666666666667, 'confidence': 1.0, 'road_closure': False}


In [ ]:
# ============================================================
# TOMTOM FLOW SEGMENT → GEODATAFRAME
# ============================================================

from shapely.geometry import LineString
import geopandas as gpd

flow_data = traffic_data["flowSegmentData"]

coords = [
    (p["longitude"], p["latitude"])
    for p in flow_data["coordinates"]["coordinate"]
]

tomtom_line = LineString(coords)

tomtom_gdf = gpd.GeoDataFrame(
    [{
        "traffic_speed_kmph": float(flow_data["currentSpeed"]),
        "free_flow_speed_kmph": float(flow_data["freeFlowSpeed"]),
        "current_travel_time_sec": float(flow_data["currentTravelTime"]),
        "free_flow_travel_time_sec": float(flow_data["freeFlowTravelTime"]),
        "confidence": float(flow_data.get("confidence", 0)),
        "road_closure": bool(flow_data.get("roadClosure", False)),
    }],
    geometry=[tomtom_line],
    crs="EPSG:4326"
)

print(tomtom_gdf)
print("\nTraffic segment length:", tomtom_line.length)

   traffic_speed_kmph  free_flow_speed_kmph  current_travel_time_sec  \
0                23.0                  23.0                    406.0   

   free_flow_travel_time_sec  confidence  road_closure  \
0                      406.0         1.0         False   

                                            geometry  
0  LINESTRING (80.27091 13.08084, 80.27091 13.080...  

Traffic segment length: 0.023569922095897474


In [ ]:
tomtom_projected = tomtom_gdf.to_crs(projected_crs)

print("TomTom geometry CRS:", tomtom_projected.crs)
print(
    "TomTom segment length (m):",
    tomtom_projected.geometry.length.iloc[0]
)

TomTom geometry CRS: EPSG:32644
TomTom segment length (m): 2587.959192887903


In [ ]:
# ============================================================
# MATCH TOMTOM FLOW SEGMENT TO OSM
# ============================================================

osm_for_traffic = osm_segments_gdf[
    [
        "osm_segment_id",
        "geometry"
    ]
].copy()

osm_for_traffic = osm_for_traffic.to_crs(projected_crs)

tomtom_match = gpd.sjoin_nearest(
    osm_for_traffic,
    tomtom_projected,
    how="left",
    max_distance=100,
    distance_col="traffic_match_m"
)

print("Matched OSM segments:", len(tomtom_match))
print(
    "Segments within 100m:",
    tomtom_match["traffic_speed_kmph"].notna().sum()
)

print(
    "\nMatch distance:"
)
print(
    tomtom_match["traffic_match_m"]
    .dropna()
    .describe()
)

Matched OSM segments: 173935
Segments within 100m: 393

Match distance:
count    393.000000
mean      35.734067
std       35.238548
min        0.000000
25%        2.542395
50%       18.074034
75%       70.629583
max       99.486196
Name: traffic_match_m, dtype: float64


In [ ]:
# ============================================================
# SELECT BEST OSM MATCH FOR THIS TOMTOM FLOW SEGMENT
# ============================================================

best_match = (
    tomtom_match
    .dropna(subset=["traffic_speed_kmph"])
    .sort_values("traffic_match_m")
    .iloc[0]
)

print("Best OSM segment:")
print("  OSM ID       :", best_match["osm_segment_id"])
print("  Match distance:", round(best_match["traffic_match_m"], 2), "m")
print("  Speed         :", best_match["traffic_speed_kmph"], "km/h")
print("  Free-flow     :", best_match["free_flow_speed_kmph"], "km/h")
print("  Travel time   :", best_match["current_travel_time_sec"], "sec")
print("  Confidence    :", best_match["confidence"])
print("  Road closure  :", best_match["road_closure"])

Best OSM segment:
  OSM ID       : 254497284_254497855_0
  Match distance: 0.0 m
  Speed         : 23.0 km/h
  Free-flow     : 23.0 km/h
  Travel time   : 406.0 sec
  Confidence    : 1.0
  Road closure  : False


In [ ]:
# ============================================================
# CREATE CLEAN TOMTOM TRAFFIC RECORD
# ============================================================

tomtom_traffic_record = {
    "osm_segment_id": best_match["osm_segment_id"],
    "traffic_speed_kmph": float(best_match["traffic_speed_kmph"]),
    "free_flow_speed_kmph": float(best_match["free_flow_speed_kmph"]),
    "congestion_ratio": (
        1.0
        - float(best_match["traffic_speed_kmph"])
        / max(float(best_match["free_flow_speed_kmph"]), 1e-6)
    ),
    "travel_time_min": float(best_match["current_travel_time_sec"]) / 60.0,
    "traffic_confidence": float(best_match["confidence"]),
    "road_closure": bool(best_match["road_closure"]),
    "traffic_match_m": float(best_match["traffic_match_m"])
}

print(tomtom_traffic_record)

{'osm_segment_id': '254497284_254497855_0', 'traffic_speed_kmph': 23.0, 'free_flow_speed_kmph': 23.0, 'congestion_ratio': 0.0, 'travel_time_min': 6.766666666666667, 'traffic_confidence': 1.0, 'road_closure': False, 'traffic_match_m': 0.0}


In [ ]:
# ============================================================
# ROUTE EDGE HELPER
# ============================================================

def get_route_edge_records(graph, route):
    records = []

    for u, v in zip(route[:-1], route[1:]):
        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        records.append({
            "u": u,
            "v": v,
            "key": key
        })

    return records


route_edges = get_route_edge_records(G, route)

print("Route nodes :", len(route))
print("Route edges :", len(route_edges))

Route nodes : 93
Route edges : 92


In [ ]:
# ============================================================
# SAMPLE TRAFFIC QUERY POINTS ALONG ROUTE
# ============================================================

import numpy as np
from shapely.geometry import Point

# Use the existing shortest route
route_nodes = route

route_edges = get_route_edge_records(G, route_nodes)

traffic_points = []

for edge in route_edges:
    u = edge["u"]
    v = edge["v"]
    key = edge["key"]

    edge_data = G.get_edge_data(u, v, key)

    if edge_data is None:
        continue

    geom = edge_data.get("geometry")

    if geom is None:
        # fallback to node coordinates
        p1 = Point(
            G.nodes[u]["x"],
            G.nodes[u]["y"]
        )
        p2 = Point(
            G.nodes[v]["x"],
            G.nodes[v]["y"]
        )
        geom = LineString([p1, p2])

    traffic_points.append(geom)

# Combine route geometry
route_geometry = gpd.GeoSeries(
    traffic_points,
    crs="EPSG:4326"
).union_all()

# Project for distance-based sampling
route_projected = gpd.GeoSeries(
    [route_geometry],
    crs="EPSG:4326"
).to_crs(projected_crs).iloc[0]

# Sample approximately every 1 km
spacing_m = 1000

distances = np.arange(
    0,
    route_projected.length,
    spacing_m
)

sample_points_projected = [
    route_projected.interpolate(float(d))
    for d in distances
]

sample_points = gpd.GeoSeries(
    sample_points_projected,
    crs=projected_crs
).to_crs("EPSG:4326")

traffic_query_points = [
    (point.y, point.x)
    for point in sample_points
]

print("Route length:", round(route_projected.length / 1000, 3), "km")
print("Traffic query points:", len(traffic_query_points))

print("\nFirst 5 points:")
for p in traffic_query_points[:5]:
    print(p)

Route length: 5.556 km
Traffic query points: 6

First 5 points:
(13.0825329, 80.2706992)
(13.0802382978533, 80.26528554586582)
(13.071927415516363, 80.26732607874675)
(13.06734297968723, 80.27316661138104)
(13.05885785199977, 80.27444133300442)


In [ ]:
# ============================================================
# FETCH TOMTOM TRAFFIC FOR ROUTE POINTS
# ============================================================

import requests
import time
import pandas as pd

traffic_results = []

for i, (lat, lon) in enumerate(traffic_query_points):

    url = (
        "https://api.tomtom.com/"
        "traffic/services/4/flowSegmentData/"
        "absolute/10/json"
    )

    params = {
        "point": f"{lat},{lon}",
        "unit": "KMPH",
        "openLr": "false",
        "key": TOMTOM_API_KEY
    }

    try:
        response = requests.get(
            url,
            params=params,
            timeout=20
        )

        response.raise_for_status()

        data = response.json()["flowSegmentData"]

        current_speed = float(data["currentSpeed"])
        free_flow_speed = float(data["freeFlowSpeed"])

        congestion_ratio = (
            1 - current_speed / free_flow_speed
            if free_flow_speed > 0
            else 0.0
        )

        traffic_results.append({
            "query_index": i,
            "latitude": lat,
            "longitude": lon,
            "traffic_speed_kmph": current_speed,
            "free_flow_speed_kmph": free_flow_speed,
            "congestion_ratio": max(
                0.0,
                min(1.0, congestion_ratio)
            ),
            "travel_time_min": (
                float(data["currentTravelTime"]) / 60.0
            ),
            "confidence": float(
                data.get("confidence", 0)
            ),
            "road_closure": bool(
                data.get("roadClosure", False)
            )
        })

        print(
            f"{i+1}/{len(traffic_query_points)} → "
            f"{current_speed:.1f} km/h | "
            f"Free: {free_flow_speed:.1f} km/h | "
            f"Congestion: {congestion_ratio:.2f}"
        )

    except Exception as e:
        print(f"{i+1}/{len(traffic_query_points)} → ERROR: {e}")

    time.sleep(0.2)

traffic_df = pd.DataFrame(traffic_results)

print("\nTotal successful traffic queries:", len(traffic_df))

display(traffic_df)

1/6 → 23.0 km/h | Free: 23.0 km/h | Congestion: 0.00
2/6 → 28.0 km/h | Free: 28.0 km/h | Congestion: 0.00
3/6 → 27.0 km/h | Free: 27.0 km/h | Congestion: 0.00
4/6 → 30.0 km/h | Free: 30.0 km/h | Congestion: 0.00
5/6 → 20.0 km/h | Free: 20.0 km/h | Congestion: 0.00
6/6 → 32.0 km/h | Free: 32.0 km/h | Congestion: 0.00

Total successful traffic queries: 6


,query_index,latitude,longitude,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,travel_time_min,confidence,road_closure
0,0,13.082533,80.270699,23.0,23.0,0.0,6.766667,1.0,False
1,1,13.080238,80.265286,28.0,28.0,0.0,0.533333,1.0,False
2,2,13.071927,80.267326,27.0,27.0,0.0,2.116667,1.0,False
3,3,13.067343,80.273167,30.0,30.0,0.0,2.800000,1.0,False
4,4,13.058858,80.274441,20.0,20.0,0.0,8.400000,1.0,False
5,5,13.053794,80.279323,32.0,32.0,0.0,24.033333,1.0,False


In [ ]:
# ============================================================
# MATCH TOMTOM TRAFFIC POINTS → OSM ROAD SEGMENTS
# ============================================================

traffic_points_gdf = gpd.GeoDataFrame(
    traffic_df.copy(),
    geometry=[
        Point(lon, lat)
        for lon, lat in zip(
            traffic_df["longitude"],
            traffic_df["latitude"]
        )
    ],
    crs="EPSG:4326"
)

traffic_points_projected = traffic_points_gdf.to_crs(projected_crs)

osm_for_traffic = osm_segments_gdf[
    ["osm_segment_id", "geometry"]
].copy()

osm_for_traffic = osm_for_traffic.to_crs(projected_crs)

traffic_osm_match = gpd.sjoin_nearest(
    traffic_points_projected,
    osm_for_traffic,
    how="left",
    distance_col="traffic_match_m"
)

traffic_osm_match = traffic_osm_match[
    traffic_osm_match["traffic_match_m"] <= 100
].copy()

print("Traffic points:", len(traffic_df))
print("Matched OSM segments:", len(traffic_osm_match))

display(
    traffic_osm_match[
        [
            "query_index",
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "traffic_match_m"
        ]
    ]
)

Traffic points: 6
Matched OSM segments: 9


,query_index,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,traffic_match_m
0,0,258915883_254497595_0,23.0,23.0,0.0,0.000000e+00
0,0,254497596_254497595_0,23.0,23.0,0.0,0.000000e+00
0,0,254497595_254497596_0,23.0,23.0,0.0,0.000000e+00
0,0,254497595_254497640_0,23.0,23.0,0.0,0.000000e+00
1,1,2197652486_10942180788_0,28.0,28.0,0.0,4.170177e-10
2,2,266204402_248468824_0,27.0,27.0,0.0,2.890459e-10
3,3,2482072912_2214509300_0,30.0,30.0,0.0,5.361399e-10
4,4,247874843_259209328_0,20.0,20.0,0.0,1.534284e-10
5,5,259058214_259058188_0,32.0,32.0,0.0,5.832785e-10


In [ ]:
# ============================================================
# TRAFFIC LOOKUP BY OSM SEGMENT
# ============================================================

traffic_lookup = {}

for _, row in traffic_osm_match.iterrows():

    osm_id = row["osm_segment_id"]

    traffic_lookup[osm_id] = {
        "traffic_speed_kmph": float(
            row["traffic_speed_kmph"]
        ),
        "free_flow_speed_kmph": float(
            row["free_flow_speed_kmph"]
        ),
        "congestion_ratio": float(
            row["congestion_ratio"]
        ),
        "travel_time_min": float(
            row["travel_time_min"]
        ),
        "traffic_confidence": float(
            row["confidence"]
        ),
        "road_closure": bool(
            row["road_closure"]
        ),
        "traffic_match_m": float(
            row["traffic_match_m"]
        )
    }

print("Traffic lookup entries:", len(traffic_lookup))

Traffic lookup entries: 9


In [ ]:
# ============================================================
# INTEGRATE TOMTOM TRAFFIC INTO OSM ML DATA
# ============================================================

traffic_columns = [
    "traffic_speed_kmph",
    "free_flow_speed_kmph",
    "congestion_ratio",
    "travel_time_min"
]

# Remove old traffic values if they exist
osm_ml = osm_ml.drop(
    columns=traffic_columns,
    errors="ignore"
)

# Create traffic dataframe
traffic_features_osm = traffic_osm_match[
    [
        "osm_segment_id",
        "traffic_speed_kmph",
        "free_flow_speed_kmph",
        "congestion_ratio",
        "travel_time_min"
    ]
].copy()

# If multiple TomTom points map to the same OSM segment,
# keep the first/closest observation
traffic_features_osm = (
    traffic_features_osm
    .drop_duplicates("osm_segment_id")
)

# Merge
osm_ml = osm_ml.merge(
    traffic_features_osm,
    on="osm_segment_id",
    how="left"
)

print("OSM segments:", len(osm_ml))
print(
    "Segments with live TomTom traffic:",
    osm_ml["traffic_speed_kmph"].notna().sum()
)

display(
    osm_ml[
        [
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "travel_time_min"
        ]
    ]
    .dropna()
    .head(10)
)

OSM segments: 173954
Segments with live TomTom traffic: 9


,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,travel_time_min
993,247874843_259209328_0,20.0,20.0,0.0,8.400000
4620,254497595_254497596_0,23.0,23.0,0.0,6.766667
4621,254497595_254497640_0,23.0,23.0,0.0,6.766667
4622,254497596_254497595_0,23.0,23.0,0.0,6.766667
6757,258915883_254497595_0,23.0,23.0,0.0,6.766667
8177,259058214_259058188_0,32.0,32.0,0.0,24.033333
12132,266204402_248468824_0,27.0,27.0,0.0,2.116667
77742,2197652486_10942180788_0,28.0,28.0,0.0,0.533333
85882,2482072912_2214509300_0,30.0,30.0,0.0,2.800000


In [ ]:
# ============================================================
# TRAFFIC RISK 0–100
# ============================================================

osm_ml["traffic_risk_100"] = (
    osm_ml["congestion_ratio"]
    .fillna(0.0)
    .clip(0, 1)
    * 100
)

print(
    osm_ml["traffic_risk_100"]
    .describe()
)

count    173954.0
mean          0.0
std           0.0
min           0.0
25%           0.0
50%           0.0
75%           0.0
max           0.0
Name: traffic_risk_100, dtype: float64


In [ ]:
# ============================================================
# REMOVE DUPLICATE OSM SEGMENTS CREATED BY TRAFFIC MERGE
# ============================================================

print("Before cleanup:", len(osm_ml))

osm_ml = (
    osm_ml
    .sort_values("osm_segment_id")
    .drop_duplicates(
        subset="osm_segment_id",
        keep="first"
    )
    .reset_index(drop=True)
)

print("After cleanup:", len(osm_ml))

print(
    "Unique OSM segment IDs:",
    osm_ml["osm_segment_id"].nunique()
)

Before cleanup: 173954
After cleanup: 173935
Unique OSM segment IDs: 173935


In [ ]:
# ============================================================
# DISTINGUISH OBSERVED VS UNOBSERVED TRAFFIC
# ============================================================

osm_ml["traffic_observed"] = (
    osm_ml["traffic_speed_kmph"].notna()
)

print(
    "Observed traffic segments:",
    osm_ml["traffic_observed"].sum()
)

print(
    "Unobserved traffic segments:",
    (~osm_ml["traffic_observed"]).sum()
)

Observed traffic segments: 9
Unobserved traffic segments: 173926


In [ ]:
# ============================================================
# TRAFFIC DATA VALIDATION
# ============================================================

observed_traffic = osm_ml[
    osm_ml["traffic_observed"]
].copy()

print("Observed segments:", len(observed_traffic))

display(
    observed_traffic[
        [
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "traffic_risk_100",
            "traffic_observed"
        ]
    ]
)

Observed segments: 9


,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,traffic_risk_100,traffic_observed
47929,2197652486_10942180788_0,28.0,28.0,0.0,0.0,True
56770,247874843_259209328_0,20.0,20.0,0.0,0.0,True
57081,2482072912_2214509300_0,30.0,30.0,0.0,0.0,True
60572,254497595_254497596_0,23.0,23.0,0.0,0.0,True
60573,254497595_254497640_0,23.0,23.0,0.0,0.0,True
60574,254497596_254497595_0,23.0,23.0,0.0,0.0,True
62738,258915883_254497595_0,23.0,23.0,0.0,0.0,True
64157,259058214_259058188_0,32.0,32.0,0.0,0.0,True
68189,266204402_248468824_0,27.0,27.0,0.0,0.0,True


In [ ]:
# ============================================================
# FINAL TRAFFIC LOOKUP
# ============================================================

traffic_lookup = {}

for _, row in osm_ml[
    osm_ml["traffic_observed"]
].iterrows():

    traffic_lookup[row["osm_segment_id"]] = {
        "traffic_speed_kmph": float(
            row["traffic_speed_kmph"]
        ),
        "free_flow_speed_kmph": float(
            row["free_flow_speed_kmph"]
        ),
        "congestion_ratio": float(
            row["congestion_ratio"]
        ),
        "traffic_risk_100": float(
            row["traffic_risk_100"]
        ),
        "travel_time_min": float(
            row["travel_time_min"]
        ),
        "confidence": 1.0
    }

print("Traffic lookup size:", len(traffic_lookup))

Traffic lookup size: 9


In [ ]:
# ============================================================
# CHECK TRAFFIC COVERAGE OF CANDIDATE ROUTES
# ============================================================

for i, candidate_route in enumerate(candidate_routes):

    edge_records = get_route_edge_records(
        G,
        candidate_route
    )

    route_segment_ids = [
        f"{e['u']}_{e['v']}_{e['key']}"
        for e in edge_records
    ]

    observed = [
        sid for sid in route_segment_ids
        if sid in traffic_lookup
    ]

    print(
        f"Route {i+1}: "
        f"{len(observed)}/{len(route_segment_ids)} "
        f"segments have live traffic"
    )

Route 1: 1/36 segments have live traffic
Route 2: 1/37 segments have live traffic
Route 3: 1/38 segments have live traffic
Route 4: 1/38 segments have live traffic
Route 5: 1/39 segments have live traffic
Route 6: 1/39 segments have live traffic
Route 7: 1/40 segments have live traffic
Route 8: 4/88 segments have live traffic
Route 9: 4/88 segments have live traffic
Route 10: 5/91 segments have live traffic
Route 11: 4/92 segments have live traffic
Route 12: 4/89 segments have live traffic
Route 13: 4/85 segments have live traffic
Route 14: 4/92 segments have live traffic
Route 15: 4/89 segments have live traffic
Route 16: 4/85 segments have live traffic
Route 17: 1/40 segments have live traffic
Route 18: 4/89 segments have live traffic
Route 19: 5/95 segments have live traffic
Route 20: 5/92 segments have live traffic


In [ ]:
# ============================================================
# GENERATE TRAFFIC QUERY POINTS FOR CANDIDATE ROUTES
# ============================================================

import numpy as np
import geopandas as gpd
from shapely.geometry import Point, LineString

def build_route_geometry(graph, route_nodes):
    """Build a LineString from an OSM route."""

    geometries = []

    for u, v in zip(route_nodes[:-1], route_nodes[1:]):

        edge_data = graph.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        data = edge_data[key]

        if data.get("geometry") is not None:
            geometries.append(data["geometry"])
        else:
            geometries.append(
                LineString([
                    (
                        graph.nodes[u]["x"],
                        graph.nodes[u]["y"]
                    ),
                    (
                        graph.nodes[v]["x"],
                        graph.nodes[v]["y"]
                    )
                ])
            )

    return gpd.GeoSeries(
        geometries,
        crs="EPSG:4326"
    ).union_all()


# ------------------------------------------------------------
# Generate points
# ------------------------------------------------------------

candidate_traffic_points = []

spacing_m = 500

for route_idx, candidate_route in enumerate(candidate_routes):

    route_geom = build_route_geometry(
        G,
        candidate_route
    )

    route_projected = gpd.GeoSeries(
        [route_geom],
        crs="EPSG:4326"
    ).to_crs(projected_crs).iloc[0]

    distances = np.arange(
        0,
        route_projected.length,
        spacing_m
    )

    # Also include route endpoint
    if len(distances) == 0 or distances[-1] < route_projected.length:
        distances = np.append(
            distances,
            route_projected.length
        )

    for distance in distances:

        point_projected = route_projected.interpolate(
            float(distance)
        )

        point = gpd.GeoSeries(
            [point_projected],
            crs=projected_crs
        ).to_crs("EPSG:4326").iloc[0]

        candidate_traffic_points.append({
            "route_index": route_idx,
            "distance_from_start_m": float(distance),
            "latitude": point.y,
            "longitude": point.x
        })


candidate_traffic_points_df = pd.DataFrame(
    candidate_traffic_points
)

print(
    "Candidate routes:",
    candidate_traffic_points_df["route_index"].nunique()
)

print(
    "Total traffic query points:",
    len(candidate_traffic_points_df)
)

display(
    candidate_traffic_points_df.head(15)
)

Candidate routes: 20
Total traffic query points: 255


,route_index,distance_from_start_m,latitude,longitude
0,0,0.000000,13.082533,80.270699
1,0,500.000000,13.081374,80.272700
2,0,1000.000000,13.082015,80.277246
3,0,1500.000000,13.082271,80.281779
4,0,2000.000000,13.078665,80.282356
5,0,2500.000000,13.075024,80.284981
6,0,3000.000000,13.071058,80.285095
7,0,3500.000000,13.066648,80.284097
8,0,4000.000000,13.062256,80.283012
9,0,4500.000000,13.057823,80.282107


In [ ]:
# ============================================================
# DEDUPLICATE TRAFFIC QUERY POINTS
# ============================================================

traffic_points_gdf = gpd.GeoDataFrame(
    candidate_traffic_points_df.copy(),
    geometry=[
        Point(lon, lat)
        for lon, lat in zip(
            candidate_traffic_points_df["longitude"],
            candidate_traffic_points_df["latitude"]
        )
    ],
    crs="EPSG:4326"
)

traffic_points_projected = traffic_points_gdf.to_crs(
    projected_crs
)

# Keep track of which points are already represented
selected_indices = []

for idx, point in enumerate(
    traffic_points_projected.geometry
):

    if not selected_indices:
        selected_indices.append(idx)
        continue

    selected_points = traffic_points_projected.geometry.iloc[
        selected_indices
    ]

    distances = selected_points.distance(point)

    if distances.min() >= 100:
        selected_indices.append(idx)


unique_traffic_points = (
    traffic_points_gdf
    .iloc[selected_indices]
    .copy()
    .reset_index(drop=True)
)

print(
    "Original query points:",
    len(traffic_points_gdf)
)

print(
    "Unique query points:",
    len(unique_traffic_points)
)

print(
    "API calls saved:",
    len(traffic_points_gdf)
    - len(unique_traffic_points)
)

display(
    unique_traffic_points.head(15)
)

Original query points: 255
Unique query points: 35
API calls saved: 220


,route_index,distance_from_start_m,latitude,longitude,geometry
0,0,0.000000,13.082533,80.270699,POINT (80.2707 13.08253)
1,0,500.000000,13.081374,80.272700,POINT (80.2727 13.08137)
2,0,1000.000000,13.082015,80.277246,POINT (80.27725 13.08202)
3,0,1500.000000,13.082271,80.281779,POINT (80.28178 13.08227)
4,0,2000.000000,13.078665,80.282356,POINT (80.28236 13.07866)
5,0,2500.000000,13.075024,80.284981,POINT (80.28498 13.07502)
6,0,3000.000000,13.071058,80.285095,POINT (80.2851 13.07106)
7,0,3500.000000,13.066648,80.284097,POINT (80.2841 13.06665)
8,0,4000.000000,13.062256,80.283012,POINT (80.28301 13.06226)
9,0,4500.000000,13.057823,80.282107,POINT (80.28211 13.05782)


In [ ]:
# ============================================================
# ASSIGN TRAFFIC QUERY IDs
# ============================================================

unique_traffic_points["traffic_query_id"] = range(
    len(unique_traffic_points)
)

print(
    "Final TomTom query count:",
    len(unique_traffic_points)
)

display(
    unique_traffic_points[
        [
            "traffic_query_id",
            "latitude",
            "longitude"
        ]
    ].head(20)
)

Final TomTom query count: 35


,traffic_query_id,latitude,longitude
0,0,13.082533,80.270699
1,1,13.081374,80.272700
2,2,13.082015,80.277246
3,3,13.082271,80.281779
4,4,13.078665,80.282356
5,5,13.075024,80.284981
6,6,13.071058,80.285095
7,7,13.066648,80.284097
8,8,13.062256,80.283012
9,9,13.057823,80.282107


In [ ]:
# ============================================================
# FETCH TOMTOM TRAFFIC FOR UNIQUE ROUTE POINTS
# ============================================================

import requests
import time
import pandas as pd

traffic_batch_results = []

for _, row in unique_traffic_points.iterrows():

    query_id = int(row["traffic_query_id"])
    lat = float(row["latitude"])
    lon = float(row["longitude"])

    url = (
        "https://api.tomtom.com/"
        "traffic/services/4/flowSegmentData/"
        "absolute/10/json"
    )

    params = {
        "point": f"{lat},{lon}",
        "unit": "KMPH",
        "openLr": "false",
        "key": TOMTOM_API_KEY
    }

    try:
        response = requests.get(
            url,
            params=params,
            timeout=20
        )

        response.raise_for_status()

        data = response.json()["flowSegmentData"]

        current_speed = float(data["currentSpeed"])
        free_flow_speed = float(data["freeFlowSpeed"])

        congestion_ratio = (
            1.0 - current_speed / free_flow_speed
            if free_flow_speed > 0
            else 0.0
        )

        traffic_batch_results.append({
            "traffic_query_id": query_id,
            "latitude": lat,
            "longitude": lon,
            "traffic_speed_kmph": current_speed,
            "free_flow_speed_kmph": free_flow_speed,
            "congestion_ratio": max(
                0.0,
                min(1.0, congestion_ratio)
            ),
            "travel_time_min": (
                float(data["currentTravelTime"]) / 60.0
            ),
            "confidence": float(
                data.get("confidence", 0)
            ),
            "road_closure": bool(
                data.get("roadClosure", False)
            )
        })

        print(
            f"{query_id:02d} | "
            f"{current_speed:.1f} km/h | "
            f"free {free_flow_speed:.1f} km/h | "
            f"congestion {congestion_ratio:.3f}"
        )

    except Exception as e:

        print(
            f"{query_id:02d} | ERROR | {e}"
        )

    time.sleep(0.2)


traffic_batch_df = pd.DataFrame(
    traffic_batch_results
)

print("\n--------------------------------")
print(
    "Successful TomTom queries:",
    len(traffic_batch_df)
)
print(
    "Failed queries:",
    len(unique_traffic_points)
    - len(traffic_batch_df)
)

display(traffic_batch_df)

00 | 23.0 km/h | free 23.0 km/h | congestion 0.000
01 | 31.0 km/h | free 31.0 km/h | congestion 0.000
02 | 31.0 km/h | free 31.0 km/h | congestion 0.000
03 | 30.0 km/h | free 32.0 km/h | congestion 0.062
04 | 32.0 km/h | free 32.0 km/h | congestion 0.000
05 | 34.0 km/h | free 34.0 km/h | congestion 0.000
06 | 42.0 km/h | free 42.0 km/h | congestion 0.000
07 | 42.0 km/h | free 42.0 km/h | congestion 0.000
08 | 32.0 km/h | free 32.0 km/h | congestion 0.000
09 | 32.0 km/h | free 32.0 km/h | congestion 0.000
10 | 33.0 km/h | free 33.0 km/h | congestion 0.000
11 | 33.0 km/h | free 33.0 km/h | congestion 0.000
12 | 31.0 km/h | free 31.0 km/h | congestion 0.000
13 | 31.0 km/h | free 31.0 km/h | congestion 0.000
14 | 30.0 km/h | free 32.0 km/h | congestion 0.062
15 | 32.0 km/h | free 32.0 km/h | congestion 0.000
16 | 42.0 km/h | free 42.0 km/h | congestion 0.000
17 | 42.0 km/h | free 42.0 km/h | congestion 0.000
18 | 32.0 km/h | free 32.0 km/h | congestion 0.000
19 | 32.0 km/h | free 32.0 km/h

,traffic_query_id,latitude,longitude,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,travel_time_min,confidence,road_closure
0,0,13.082533,80.270699,23.0,23.0,0.000000,6.766667,1.000000,False
1,1,13.081374,80.272700,31.0,31.0,0.000000,26.416667,1.000000,False
2,2,13.082015,80.277246,31.0,31.0,0.000000,26.416667,1.000000,False
3,3,13.082271,80.281779,30.0,32.0,0.062500,23.366667,0.962388,True
4,4,13.078665,80.282356,32.0,32.0,0.000000,24.033333,1.000000,False
5,5,13.075024,80.284981,34.0,34.0,0.000000,24.633333,1.000000,False
6,6,13.071058,80.285095,42.0,42.0,0.000000,1.466667,1.000000,False
7,7,13.066648,80.284097,42.0,42.0,0.000000,1.466667,1.000000,False
8,8,13.062256,80.283012,32.0,32.0,0.000000,24.033333,1.000000,False
9,9,13.057823,80.282107,32.0,32.0,0.000000,24.033333,1.000000,False


In [ ]:
# ============================================================
# VALIDATE TOMTOM RESULTS
# ============================================================

print("Traffic speed:")
print(
    traffic_batch_df[
        "traffic_speed_kmph"
    ].describe()
)

print("\nCongestion:")
print(
    traffic_batch_df[
        "congestion_ratio"
    ].describe()
)

print(
    "\nRoad closures:",
    traffic_batch_df["road_closure"].sum()
)

print(
    "Average confidence:",
    traffic_batch_df["confidence"].mean()
)

Traffic speed:
count    35.000000
mean     30.342857
std       6.009516
min      17.000000
25%      28.000000
50%      31.000000
75%      32.000000
max      42.000000
Name: traffic_speed_kmph, dtype: float64

Congestion:
count    35.000000
mean      0.005159
std       0.017122
min       0.000000
25%       0.000000
50%       0.000000
75%       0.000000
max       0.062500
Name: congestion_ratio, dtype: float64

Road closures: 3
Average confidence: 0.9951548285714286


In [ ]:
# ============================================================
# MATCH 35 TOMTOM OBSERVATIONS → OSM SEGMENTS
# ============================================================

traffic_points_gdf = gpd.GeoDataFrame(
    traffic_batch_df.copy(),
    geometry=[
        Point(lon, lat)
        for lon, lat in zip(
            traffic_batch_df["longitude"],
            traffic_batch_df["latitude"]
        )
    ],
    crs="EPSG:4326"
)

traffic_points_projected = traffic_points_gdf.to_crs(
    projected_crs
)

osm_for_traffic = osm_segments_gdf[
    ["osm_segment_id", "geometry"]
].copy().to_crs(projected_crs)

traffic_osm_all = gpd.sjoin_nearest(
    traffic_points_projected,
    osm_for_traffic,
    how="left",
    max_distance=100,
    distance_col="traffic_match_m"
)

print("TomTom observations:", len(traffic_batch_df))
print(
    "Matched observations:",
    traffic_osm_all["osm_segment_id"].notna().sum()
)

print(
    "Unmatched observations:",
    traffic_osm_all["osm_segment_id"].isna().sum()
)

display(
    traffic_osm_all[
        [
            "traffic_query_id",
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "road_closure",
            "traffic_match_m"
        ]
    ]
)

TomTom observations: 35
Matched observations: 41
Unmatched observations: 0


,traffic_query_id,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,road_closure,traffic_match_m
0,0,258915883_254497595_0,23.0,23.0,0.000000,False,0.000000e+00
0,0,254497596_254497595_0,23.0,23.0,0.000000,False,0.000000e+00
0,0,254497595_254497596_0,23.0,23.0,0.000000,False,0.000000e+00
0,0,254497595_254497640_0,23.0,23.0,0.000000,False,0.000000e+00
1,1,10201011121_303283553_0,31.0,31.0,0.000000,False,2.991010e-11
2,2,2271477987_11936637469_0,31.0,31.0,0.000000,False,2.506283e-10
3,3,303283585_12740774712_0,30.0,32.0,0.062500,True,1.736435e-10
4,4,12740774713_12213569492_0,32.0,32.0,0.000000,False,4.674054e-10
5,5,12213569487_10536304419_0,34.0,34.0,0.000000,False,4.673189e-12
6,6,270432727_9983146260_0,42.0,42.0,0.000000,False,8.714687e-11


In [ ]:
# ============================================================
# TOMTOM TRAFFIC RISK
# ============================================================

traffic_osm_all["traffic_risk_100"] = (
    traffic_osm_all["congestion_ratio"]
    .clip(0, 1)
    * 100
)

# Strong penalty for an explicitly reported closure
traffic_osm_all.loc[
    traffic_osm_all["road_closure"] == True,
    "traffic_risk_100"
] = 100.0

display(
    traffic_osm_all[
        [
            "traffic_query_id",
            "osm_segment_id",
            "congestion_ratio",
            "traffic_risk_100",
            "road_closure",
            "confidence"
        ]
    ]
)

,traffic_query_id,osm_segment_id,congestion_ratio,traffic_risk_100,road_closure,confidence
0,0,258915883_254497595_0,0.000000,0.0,False,1.000000
0,0,254497596_254497595_0,0.000000,0.0,False,1.000000
0,0,254497595_254497596_0,0.000000,0.0,False,1.000000
0,0,254497595_254497640_0,0.000000,0.0,False,1.000000
1,1,10201011121_303283553_0,0.000000,0.0,False,1.000000
2,2,2271477987_11936637469_0,0.000000,0.0,False,1.000000
3,3,303283585_12740774712_0,0.062500,100.0,True,0.962388
4,4,12740774713_12213569492_0,0.000000,0.0,False,1.000000
5,5,12213569487_10536304419_0,0.000000,0.0,False,1.000000
6,6,270432727_9983146260_0,0.000000,0.0,False,1.000000


In [ ]:
# ============================================================
# TRAFFIC RISK SUMMARY
# ============================================================

print(
    traffic_osm_all["traffic_risk_100"].describe()
)

print(
    "\nRoad closures:",
    traffic_osm_all["road_closure"].sum()
)

print(
    "Segments with congestion:",
    (
        traffic_osm_all["congestion_ratio"] > 0
    ).sum()
)

count     41.000000
mean       7.317073
std       26.365165
min        0.000000
25%        0.000000
50%        0.000000
75%        0.000000
max      100.000000
Name: traffic_risk_100, dtype: float64

Road closures: 3
Segments with congestion: 3


In [ ]:
# ============================================================
# CONSOLIDATE TOMTOM TRAFFIC PER OSM SEGMENT
# ============================================================

traffic_osm_final = (
    traffic_osm_all
    .sort_values("traffic_match_m")
    .drop_duplicates(
        subset="osm_segment_id",
        keep="first"
    )
    .copy()
)

print(
    "TomTom observations:",
    len(traffic_osm_all)
)

print(
    "Unique OSM traffic segments:",
    len(traffic_osm_final)
)

print(
    "Duplicate OSM matches removed:",
    len(traffic_osm_all)
    - len(traffic_osm_final)
)

display(
    traffic_osm_final[
        [
            "traffic_query_id",
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "traffic_risk_100",
            "road_closure",
            "confidence",
            "traffic_match_m"
        ]
    ]
)

TomTom observations: 41
Unique OSM traffic segments: 33
Duplicate OSM matches removed: 8


,traffic_query_id,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,traffic_risk_100,road_closure,confidence,traffic_match_m
0,0,258915883_254497595_0,23.0,23.0,0.000000,0.0,False,1.000000,0.000000e+00
0,0,254497596_254497595_0,23.0,23.0,0.000000,0.0,False,1.000000,0.000000e+00
0,0,254497595_254497596_0,23.0,23.0,0.000000,0.0,False,1.000000,0.000000e+00
0,0,254497595_254497640_0,23.0,23.0,0.000000,0.0,False,1.000000,0.000000e+00
11,11,310729326_310728384_0,33.0,33.0,0.000000,0.0,False,1.000000,0.000000e+00
11,11,310728384_243066060_0,33.0,33.0,0.000000,0.0,False,1.000000,0.000000e+00
11,11,310728384_310728524_0,33.0,33.0,0.000000,0.0,False,1.000000,0.000000e+00
5,5,12213569487_10536304419_0,34.0,34.0,0.000000,0.0,False,1.000000,4.673189e-12
26,26,12486173648_11944740686_0,28.0,28.0,0.000000,0.0,False,1.000000,5.804258e-12
1,1,10201011121_303283553_0,31.0,31.0,0.000000,0.0,False,1.000000,2.991010e-11


In [ ]:
# ============================================================
# MERGE FINAL TRAFFIC FEATURES INTO OSM ML TABLE
# ============================================================

traffic_merge_cols = [
    "osm_segment_id",
    "traffic_speed_kmph",
    "free_flow_speed_kmph",
    "congestion_ratio",
    "travel_time_min",
    "traffic_risk_100",
    "road_closure",
    "confidence",
    "traffic_match_m"
]

# Remove old traffic columns
osm_ml = osm_ml.drop(
    columns=[
        c for c in traffic_merge_cols
        if c != "osm_segment_id"
    ],
    errors="ignore"
)

# Merge clean traffic data
osm_ml = osm_ml.merge(
    traffic_osm_final[traffic_merge_cols],
    on="osm_segment_id",
    how="left"
)

# Explicit observation flag
osm_ml["traffic_observed"] = (
    osm_ml["traffic_speed_kmph"].notna()
)

print("OSM rows:", len(osm_ml))
print(
    "Observed traffic:",
    osm_ml["traffic_observed"].sum()
)
print(
    "Unobserved traffic:",
    (~osm_ml["traffic_observed"]).sum()
)

OSM rows: 173935
Observed traffic: 33
Unobserved traffic: 173902


In [ ]:
# ============================================================
# CHECK ROAD CLOSURES
# ============================================================

closures = osm_ml[
    osm_ml["road_closure"] == True
].copy()

print(
    "Mapped OSM segments with closures:",
    len(closures)
)

display(
    closures[
        [
            "osm_segment_id",
            "traffic_speed_kmph",
            "free_flow_speed_kmph",
            "congestion_ratio",
            "traffic_risk_100",
            "traffic_observed"
        ]
    ]
)

Mapped OSM segments with closures: 2


,osm_segment_id,traffic_speed_kmph,free_flow_speed_kmph,congestion_ratio,traffic_risk_100,traffic_observed
56796,247874950_2218064812_0,17.0,18.0,0.055556,100.0,True
85843,303283585_12740774712_0,30.0,32.0,0.062500,100.0,True


In [ ]:
# ============================================================
# MAP LIVE TRAFFIC TO CANDIDATE ROUTE SEGMENTS
# ============================================================

# Build a GeoDataFrame containing only OSM segments
# that have actual TomTom observations.

observed_osm_traffic = osm_ml[
    osm_ml["traffic_observed"] == True
][
    [
        "osm_segment_id",
        "geometry",
        "traffic_speed_kmph",
        "free_flow_speed_kmph",
        "congestion_ratio",
        "traffic_risk_100",
        "travel_time_min",
        "road_closure"
    ]
].copy()

observed_osm_traffic = gpd.GeoDataFrame(
    observed_osm_traffic,
    geometry="geometry",
    crs="EPSG:4326"
).to_crs(projected_crs)


# ------------------------------------------------------------
# Collect all segments belonging to candidate routes
# ------------------------------------------------------------

route_segment_records = []

for route_idx, candidate_route in enumerate(candidate_routes):

    for u, v in zip(
        candidate_route[:-1],
        candidate_route[1:]
    ):

        edge_data = G.get_edge_data(u, v)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        segment_id = f"{u}_{v}_{key}"

        edge = edge_data[key]

        geometry = edge.get("geometry")

        if geometry is None:
            geometry = LineString([
                (
                    G.nodes[u]["x"],
                    G.nodes[u]["y"]
                ),
                (
                    G.nodes[v]["x"],
                    G.nodes[v]["y"]
                )
            ])

        route_segment_records.append({
            "route_index": route_idx,
            "osm_segment_id": segment_id,
            "geometry": geometry
        })


route_segments_gdf = gpd.GeoDataFrame(
    route_segment_records,
    geometry="geometry",
    crs="EPSG:4326"
).drop_duplicates(
    subset=["route_index", "osm_segment_id"]
).to_crs(projected_crs)


print(
    "Candidate-route segment records:",
    len(route_segments_gdf)
)

print(
    "Unique route/segment combinations:",
    route_segments_gdf[
        ["route_index", "osm_segment_id"]
    ].drop_duplicates().shape[0]
)

Candidate-route segment records: 1382
Unique route/segment combinations: 1382


In [ ]:
# ============================================================
# ATTACH NEAREST LIVE TOMTOM TRAFFIC
# ============================================================

route_segments_with_traffic = gpd.sjoin_nearest(
    route_segments_gdf,
    observed_osm_traffic,
    how="left",
    max_distance=250,
    distance_col="traffic_observation_distance_m"
)

# Keep only valid traffic matches
route_segments_with_traffic["traffic_observed"] = (
    route_segments_with_traffic[
        "traffic_speed_kmph"
    ].notna()
)

print(
    "Route segments:",
    len(route_segments_with_traffic)
)

print(
    "Segments with live traffic:",
    route_segments_with_traffic[
        "traffic_observed"
    ].sum()
)

print(
    "Segments without live traffic:",
    (
        ~route_segments_with_traffic[
            "traffic_observed"
        ]
    ).sum()
)

Route segments: 1783
Segments with live traffic: 1783
Segments without live traffic: 0


In [ ]:
# ============================================================
# CLEAN ROUTE ↔ LIVE TRAFFIC MATCH
# ============================================================

# Keep only the columns we actually need
observed_osm_traffic_clean = observed_osm_traffic[
    [
        "osm_segment_id",
        "geometry",
        "traffic_speed_kmph",
        "free_flow_speed_kmph",
        "congestion_ratio",
        "traffic_risk_100",
        "travel_time_min",
        "road_closure"
    ]
].copy()

# Rename to avoid ANY column collision
observed_osm_traffic_clean = observed_osm_traffic_clean.rename(
    columns={
        "osm_segment_id": "traffic_osm_segment_id"
    }
)

# Route segments only
route_segments_clean = route_segments_gdf[
    [
        "route_index",
        "osm_segment_id",
        "geometry"
    ]
].copy()

# Nearest live traffic observation
route_traffic_match = gpd.sjoin_nearest(
    route_segments_clean,
    observed_osm_traffic_clean,
    how="left",
    max_distance=100,
    distance_col="traffic_observation_distance_m"
)

# Explicit traffic observation flag
route_traffic_match["traffic_observed"] = (
    route_traffic_match[
        "traffic_osm_segment_id"
    ].notna()
)

print(
    "Route segments:",
    len(route_traffic_match)
)

print(
    "Segments with live traffic:",
    route_traffic_match["traffic_observed"].sum()
)

print(
    "Segments without live traffic:",
    (
        ~route_traffic_match["traffic_observed"]
    ).sum()
)

display(
    route_traffic_match[
        [
            "route_index",
            "osm_segment_id",
            "traffic_osm_segment_id",
            "traffic_speed_kmph",
            "congestion_ratio",
            "traffic_risk_100",
            "traffic_observation_distance_m"
        ]
    ].head(20)
)

Route segments: 1723
Segments with live traffic: 1493
Segments without live traffic: 230


,route_index,osm_segment_id,traffic_osm_segment_id,traffic_speed_kmph,congestion_ratio,traffic_risk_100,traffic_observation_distance_m
0,0,254497595_254497596_0,258915883_254497595_0,23.0,0.0,0.0,0.000000
0,0,254497595_254497596_0,254497595_254497596_0,23.0,0.0,0.0,0.000000
0,0,254497595_254497596_0,254497596_254497595_0,23.0,0.0,0.0,0.000000
0,0,254497595_254497596_0,254497595_254497640_0,23.0,0.0,0.0,0.000000
1,0,254497596_9187378785_0,254497595_254497596_0,23.0,0.0,0.0,0.000000
1,0,254497596_9187378785_0,254497596_254497595_0,23.0,0.0,0.0,0.000000
2,0,9187378785_258915889_0,258915883_254497595_0,23.0,0.0,0.0,40.635934
3,0,258915889_254497639_0,258915883_254497595_0,23.0,0.0,0.0,50.179899
4,0,254497639_258902911_0,10201011147_2197652486_0,28.0,0.0,0.0,28.686742
5,0,258902911_254497658_0,10201011147_2197652486_0,28.0,0.0,0.0,7.066707


In [ ]:
# ============================================================
# ROUTE TRAFFIC COVERAGE
# ============================================================

route_traffic_summary = (
    route_traffic_match
    .groupby("route_index")
    .agg(
        total_segments=(
            "osm_segment_id",
            "count"
        ),
        traffic_observed=(
            "traffic_observed",
            "sum"
        ),
        mean_traffic_risk=(
            "traffic_risk_100",
            "mean"
        )
    )
    .reset_index()
)

route_traffic_summary["traffic_coverage_pct"] = (
    route_traffic_summary["traffic_observed"]
    / route_traffic_summary["total_segments"]
    * 100
)

display(route_traffic_summary)

,route_index,total_segments,traffic_observed,mean_traffic_risk,traffic_coverage_pct
0,0,55,55,5.454545,100.000000
1,1,56,56,5.357143,100.000000
2,2,58,58,5.172414,100.000000
3,3,58,58,5.172414,100.000000
4,4,59,59,5.084746,100.000000
5,5,59,59,5.084746,100.000000
6,6,62,62,4.838710,100.000000
7,7,103,84,7.142857,81.553398
8,8,103,84,7.142857,81.553398
9,9,106,86,0.000000,81.132075


In [ ]:
# ============================================================
# DISTANCE-WEIGHTED TRAFFIC RISK
# ============================================================

route_traffic_match["traffic_distance_weight"] = (
    1 / (
        1
        + route_traffic_match[
            "traffic_observation_distance_m"
        ]
    )
)

# Normalize the weight within each route
route_traffic_match["traffic_distance_weight"] = (
    route_traffic_match
    .groupby("route_index")[
        "traffic_distance_weight"
    ]
    .transform(
        lambda x: x / x.sum()
    )
)

# Weighted traffic contribution
route_traffic_match["weighted_traffic_risk"] = (
    route_traffic_match["traffic_risk_100"].fillna(0)
    * route_traffic_match["traffic_distance_weight"]
)

print(
    route_traffic_match[
        [
            "route_index",
            "osm_segment_id",
            "traffic_observation_distance_m",
            "traffic_risk_100",
            "traffic_distance_weight",
            "weighted_traffic_risk"
        ]
    ].head(20)
)

    route_index             osm_segment_id  traffic_observation_distance_m  \
0             0      254497595_254497596_0                        0.000000   
0             0      254497595_254497596_0                        0.000000   
0             0      254497595_254497596_0                        0.000000   
0             0      254497595_254497596_0                        0.000000   
1             0     254497596_9187378785_0                        0.000000   
1             0     254497596_9187378785_0                        0.000000   
2             0     9187378785_258915889_0                       40.635934   
3             0      258915889_254497639_0                       50.179899   
4             0      254497639_258902911_0                       28.686742   
5             0      258902911_254497658_0                        7.066707   
6             0    254497658_10201011144_0                        7.033258   
7             0  10201011144_10201011149_0                      

In [ ]:
# ============================================================
# ROUTE TRAFFIC RISK
# ============================================================

route_traffic_risk = (
    route_traffic_match
    .groupby("route_index")
    .agg(
        traffic_risk_100=(
            "weighted_traffic_risk",
            "sum"
        ),
        traffic_observed_segments=(
            "traffic_observed",
            "sum"
        ),
        total_segments=(
            "osm_segment_id",
            "count"
        ),
        closure_segments=(
            "road_closure",
            lambda x: x.fillna(False).sum()
        )
    )
    .reset_index()
)

route_traffic_risk["traffic_coverage_pct"] = (
    route_traffic_risk["traffic_observed_segments"]
    / route_traffic_risk["total_segments"]
    * 100
)

display(route_traffic_risk)

/tmp/ipykernel_3386/2498616126.py:23: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  lambda x: x.fillna(False).sum()


,route_index,traffic_risk_100,traffic_observed_segments,total_segments,closure_segments,traffic_coverage_pct
0,0,6.458887,55,55,3,100.000000
1,1,6.453533,56,56,3,100.000000
2,2,6.449470,58,58,3,100.000000
3,3,6.067024,58,58,3,100.000000
4,4,6.444131,59,59,3,100.000000
5,5,6.062300,59,59,3,100.000000
6,6,6.442052,62,62,3,100.000000
7,7,6.555483,84,103,6,81.553398
8,8,6.514016,84,103,6,81.553398
9,9,0.000000,86,106,0,81.132075


In [ ]:
# Keep only the closest TomTom observation for each route segment
route_traffic_clean = (
    route_traffic_match
    .sort_values(
        ["route_index", "osm_segment_id", "traffic_observation_distance_m"]
    )
    .drop_duplicates(
        ["route_index", "osm_segment_id"],
        keep="first"
    )
    .copy()
)

# Traffic risk for each matched route segment
route_traffic_clean["traffic_risk_100"] = (
    route_traffic_clean["traffic_risk_100"]
    .fillna(0)
    .clip(0, 100)
)

# Distance weight: closer TomTom observations matter more
route_traffic_clean["traffic_distance_weight"] = (
    1 / (1 + route_traffic_clean["traffic_observation_distance_m"])
)

# Normalize weights within each route
route_traffic_clean["traffic_distance_weight"] = (
    route_traffic_clean
    .groupby("route_index")["traffic_distance_weight"]
    .transform(lambda x: x / x.sum())
)

# Weighted route traffic risk
route_traffic_clean["weighted_traffic_risk"] = (
    route_traffic_clean["traffic_risk_100"]
    * route_traffic_clean["traffic_distance_weight"]
)

# Aggregate
route_traffic_summary = (
    route_traffic_clean
    .groupby("route_index")
    .agg(
        traffic_risk_100=("weighted_traffic_risk", "sum"),
        traffic_observed_segments=("osm_segment_id", "count"),
        closure_segments=("road_closure", lambda x: x.fillna(False).astype(bool).sum())
    )
    .reset_index()
)

# Total route segments from candidate routes
route_segment_counts = (
    route_traffic_match
    .groupby("route_index")["osm_segment_id"]
    .nunique()
    .reset_index(name="total_segments")
)

route_traffic_summary = route_traffic_summary.merge(
    route_segment_counts,
    on="route_index",
    how="left"
)

route_traffic_summary["traffic_coverage_pct"] = (
    route_traffic_summary["traffic_observed_segments"]
    / route_traffic_summary["total_segments"]
    * 100
)

display(route_traffic_summary)

/tmp/ipykernel_3386/2410432116.py:46: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  closure_segments=("road_closure", lambda x: x.fillna(False).astype(bool).sum())
/tmp/ipykernel_3386/2410432116.py:46: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the future behavior, set `pd.set_option('future.no_silent_downcasting', True)`
  closure_segments=("road_closure", lambda x: x.fillna(False).astype(bool).sum())
/tmp/ipykernel_3386/2410432116.py:46: FutureWarning: Downcasting object dtype arrays on .fillna, .ffill, .bfill is deprecated and will change in a future version. Call result.infer_objects(copy=False) instead. To opt-in to the futur

,route_index,traffic_risk_100,traffic_observed_segments,closure_segments,total_segments,traffic_coverage_pct
0,0,7.286603,36,2,36,100.0
1,1,7.276387,37,2,37,100.0
2,2,7.274433,38,2,38,100.0
3,3,6.791717,38,2,38,100.0
4,4,7.264252,39,2,39,100.0
5,5,6.782841,39,2,39,100.0
6,6,7.267355,40,2,40,100.0
7,7,8.842948,88,6,88,100.0
8,8,8.788372,88,6,88,100.0
9,9,0.000000,91,0,91,100.0


In [ ]:
# Rebuild risk_lookup from osm_ml

risk_lookup = {
    row["osm_segment_id"]: {
        "length": float(row["length"]),
        "hybrid_risk_100": float(row["hybrid_risk_100"])
    }
    for _, row in osm_ml.iterrows()
}

# Verify
sample_key = next(iter(risk_lookup))

print("Sample segment:", sample_key)
print("Sample data:", risk_lookup[sample_key])
print("Total segments:", len(risk_lookup))

Sample segment: 10001274214_363974824_0
Sample data: {'length': 89.40515800896492, 'hybrid_risk_100': nan}
Total segments: 173935


In [ ]:
route_results = []

for i, route in enumerate(candidate_routes):

    result = score_route(G, route)

    result["route_index"] = i

    route_results.append(result)

route_results_df = pd.DataFrame(route_results)

# Add live traffic
route_results_df = route_results_df.merge(
    route_traffic_summary[
        [
            "route_index",
            "traffic_risk_100",
            "traffic_coverage_pct",
            "closure_segments"
        ]
    ],
    on="route_index",
    how="left"
)

route_results_df["traffic_risk_100"] = (
    route_results_df["traffic_risk_100"].fillna(0)
)

# Combine existing safety risk with live traffic
route_results_df["final_route_risk"] = (
    0.90 * route_results_df["route_risk"]
    + 0.10 * route_results_df["traffic_risk_100"]
)

route_results_df["final_safety_score"] = (
    100 - route_results_df["final_route_risk"]
)

route_results_df = (
    route_results_df
    .sort_values("final_safety_score", ascending=False)
    .reset_index(drop=True)
)

display(
    route_results_df[
        [
            "route_index",
            "distance_km",
            "route_risk",
            "traffic_risk_100",
            "traffic_coverage_pct",
            "closure_segments",
            "final_route_risk",
            "final_safety_score"
        ]
    ]
)

,route_index,distance_km,route_risk,traffic_risk_100,traffic_coverage_pct,closure_segments,final_route_risk,final_safety_score
0,19,5.571968,62.227334,0.000000,100.0,0,56.004601,43.995399
1,9,5.564761,62.228049,0.000000,100.0,0,56.005244,43.994756
2,18,5.571863,62.228574,0.000000,100.0,0,56.005717,43.994283
3,17,5.571743,62.238811,8.350870,100.0,6,56.850017,43.149983
4,14,5.567973,62.236649,8.748095,100.0,6,56.887794,43.112206
5,13,5.567869,62.237890,8.744166,100.0,6,56.888518,43.111482
6,15,5.569446,62.238026,8.759343,100.0,5,56.890157,43.109843
7,8,5.560767,62.237377,8.788372,100.0,6,56.892476,43.107524
8,11,5.565910,62.237935,8.802445,100.0,6,56.894386,43.105614
9,10,5.565805,62.239177,8.798494,100.0,6,56.895108,43.104892


In [ ]:
# Use the existing candidate route scores and add live TomTom traffic

route_results_df = pd.DataFrame([
    {
        "route_index": i,
        **score_route(G, route)
    }
    for i, route in enumerate(candidate_routes)
])

# Add live traffic
route_results_df = route_results_df.merge(
    route_traffic_summary[
        [
            "route_index",
            "traffic_risk_100",
            "traffic_coverage_pct",
            "closure_segments"
        ]
    ],
    on="route_index",
    how="left"
)

route_results_df["traffic_risk_100"] = (
    route_results_df["traffic_risk_100"].fillna(0)
)

# Combine existing route risk with live traffic
route_results_df["final_route_risk"] = (
    0.90 * route_results_df["route_risk"]
    + 0.10 * route_results_df["traffic_risk_100"]
)

route_results_df["final_safety_score"] = (
    100 - route_results_df["final_route_risk"]
)

route_results_df = (
    route_results_df
    .sort_values("final_safety_score", ascending=False)
    .reset_index(drop=True)
)

display(
    route_results_df[
        [
            "route_index",
            "distance_km",
            "route_risk",
            "traffic_risk_100",
            "traffic_coverage_pct",
            "closure_segments",
            "final_route_risk",
            "final_safety_score"
        ]
    ]
)

,route_index,distance_km,route_risk,traffic_risk_100,traffic_coverage_pct,closure_segments,final_route_risk,final_safety_score
0,19,5.571968,62.227334,0.000000,100.0,0,56.004601,43.995399
1,9,5.564761,62.228049,0.000000,100.0,0,56.005244,43.994756
2,18,5.571863,62.228574,0.000000,100.0,0,56.005717,43.994283
3,17,5.571743,62.238811,8.350870,100.0,6,56.850017,43.149983
4,14,5.567973,62.236649,8.748095,100.0,6,56.887794,43.112206
5,13,5.567869,62.237890,8.744166,100.0,6,56.888518,43.111482
6,15,5.569446,62.238026,8.759343,100.0,5,56.890157,43.109843
7,8,5.560767,62.237377,8.788372,100.0,6,56.892476,43.107524
8,11,5.565910,62.237935,8.802445,100.0,6,56.894386,43.105614
9,10,5.565805,62.239177,8.798494,100.0,6,56.895108,43.104892


In [ ]:
# Add actual observed traffic segment counts

traffic_counts = route_traffic_summary[
    [
        "route_index",
        "traffic_observed_segments"
    ]
].copy()

route_results_df = route_results_df.drop(
    columns=[
        "traffic_observed_segments",
        "total_route_segments",
        "traffic_coverage_pct"
    ],
    errors="ignore"
)

route_results_df = route_results_df.merge(
    traffic_counts,
    on="route_index",
    how="left"
)

# Actual number of OSM segments in each route
route_results_df["total_route_segments"] = (
    route_results_df["route_index"]
    .map({
        i: len(route) - 1
        for i, route in enumerate(candidate_routes)
    })
)

# True TomTom coverage
route_results_df["traffic_coverage_pct"] = (
    route_results_df["traffic_observed_segments"]
    / route_results_df["total_route_segments"]
    * 100
)

display(
    route_results_df[
        [
            "route_index",
            "distance_km",
            "route_risk",
            "traffic_risk_100",
            "traffic_observed_segments",
            "total_route_segments",
            "traffic_coverage_pct",
            "closure_segments",
            "final_route_risk",
            "final_safety_score"
        ]
    ]
    .sort_values("final_safety_score", ascending=False)
    .reset_index(drop=True)
)

,route_index,distance_km,route_risk,traffic_risk_100,traffic_observed_segments,total_route_segments,traffic_coverage_pct,closure_segments,final_route_risk,final_safety_score
0,19,5.571968,62.227334,0.000000,92,92,100.0,0,56.004601,43.995399
1,9,5.564761,62.228049,0.000000,91,91,100.0,0,56.005244,43.994756
2,18,5.571863,62.228574,0.000000,95,95,100.0,0,56.005717,43.994283
3,17,5.571743,62.238811,8.350870,89,89,100.0,6,56.850017,43.149983
4,14,5.567973,62.236649,8.748095,89,89,100.0,6,56.887794,43.112206
5,13,5.567869,62.237890,8.744166,92,92,100.0,6,56.888518,43.111482
6,15,5.569446,62.238026,8.759343,85,85,100.0,5,56.890157,43.109843
7,8,5.560767,62.237377,8.788372,88,88,100.0,6,56.892476,43.107524
8,11,5.565910,62.237935,8.802445,89,89,100.0,6,56.894386,43.105614
9,10,5.565805,62.239177,8.798494,92,92,100.0,6,56.895108,43.104892


In [ ]:
# Select the top 5 routes based on final safety score

top_5_routes = (
    route_results_df
    .sort_values("final_safety_score", ascending=False)
    .head(5)
    .copy()
)

top_5_routes["rank"] = range(1, len(top_5_routes) + 1)

top_5_routes = top_5_routes[
    [
        "rank",
        "route_index",
        "distance_km",
        "route_risk",
        "traffic_risk_100",
        "closure_segments",
        "final_route_risk",
        "final_safety_score"
    ]
]

display(top_5_routes)

,rank,route_index,distance_km,route_risk,traffic_risk_100,closure_segments,final_route_risk,final_safety_score
0,1,19,5.571968,62.227334,0.000000,0,56.004601,43.995399
1,2,9,5.564761,62.228049,0.000000,0,56.005244,43.994756
2,3,18,5.571863,62.228574,0.000000,0,56.005717,43.994283
3,4,17,5.571743,62.238811,8.350870,6,56.850017,43.149983
4,5,14,5.567973,62.236649,8.748095,6,56.887794,43.112206


In [ ]:
import folium

# Chennai map center
m = folium.Map(
    location=[13.0827, 80.2707],
    zoom_start=13,
    tiles="Esri.WorldStreetMap"
)

# Route colors
route_colors = [
    "red",
    "blue",
    "green",
    "purple",
    "orange"
]

for _, row in top_5_routes.iterrows():

    route_index = int(row["route_index"])
    rank = int(row["rank"])

    route = candidate_routes[route_index]

    # Convert OSM nodes to latitude/longitude
    route_coords = [
        (G.nodes[node]["y"], G.nodes[node]["x"])
        for node in route
    ]

    popup_text = f"""
    <b>Rank:</b> {rank}<br>
    <b>Route:</b> {route_index}<br>
    <b>Distance:</b> {row["distance_km"]:.3f} km<br>
    <b>Safety Score:</b> {row["final_safety_score"]:.2f}<br>
    <b>Route Risk:</b> {row["route_risk"]:.2f}<br>
    <b>Traffic Risk:</b> {row["traffic_risk_100"]:.2f}<br>
    <b>Closures:</b> {int(row["closure_segments"])}
    """

    folium.PolyLine(
        route_coords,
        color=route_colors[rank - 1],
        weight=6,
        opacity=0.8,
        popup=folium.Popup(popup_text, max_width=300),
        tooltip=f"Rank {rank} | Safety Score {row['final_safety_score']:.2f}"
    ).add_to(m)

# Start marker
folium.Marker(
    [13.0827, 80.2707],
    popup="Start: Chennai Central",
    icon=folium.Icon(icon="play", prefix="fa")
).add_to(m)

# Destination marker
folium.Marker(
    [13.0500, 80.2824],
    popup="Destination: Marina Beach",
    icon=folium.Icon(icon="flag", prefix="fa")
).add_to(m)

display(m)

In [ ]:
import math

def get_bearing(lat1, lon1, lat2, lon2):
    """
    Calculate bearing between two geographic points.
    """
    lat1 = math.radians(lat1)
    lat2 = math.radians(lat2)
    diff_lon = math.radians(lon2 - lon1)

    x = math.sin(diff_lon) * math.cos(lat2)
    y = (
        math.cos(lat1) * math.sin(lat2)
        - math.sin(lat1) * math.cos(lat2) * math.cos(diff_lon)
    )

    bearing = math.degrees(math.atan2(x, y))
    return (bearing + 360) % 360


def bearing_to_direction(bearing):
    directions = [
        "North",
        "North-East",
        "East",
        "South-East",
        "South",
        "South-West",
        "West",
        "North-West"
    ]

    index = int((bearing + 22.5) // 45) % 8
    return directions[index]


def generate_route_instructions(route):
    instructions = []

    for i in range(len(route) - 1):

        node1 = route[i]
        node2 = route[i + 1]

        lat1 = G.nodes[node1]["y"]
        lon1 = G.nodes[node1]["x"]

        lat2 = G.nodes[node2]["y"]
        lon2 = G.nodes[node2]["x"]

        edge_data = G.get_edge_data(node1, node2)

        if edge_data is None:
            continue

        key = min(
            edge_data,
            key=lambda k: edge_data[k].get(
                "length",
                float("inf")
            )
        )

        edge = edge_data[key]

        distance_m = float(
            edge.get("length", 0)
        )

        bearing = get_bearing(
            lat1,
            lon1,
            lat2,
            lon2
        )

        direction = bearing_to_direction(bearing)

        road_name = edge.get("name")

        if isinstance(road_name, list):
            road_name = road_name[0]

        if not road_name:
            road_name = "Unnamed road"

        instructions.append({
            "step": i + 1,
            "road": road_name,
            "direction": direction,
            "distance_m": round(distance_m, 1),
            "latitude": lat2,
            "longitude": lon2
        })

    return instructions


# Generate instructions for Top 5
top5_instructions = {}

for _, row in top_5_routes.iterrows():

    rank = int(row["rank"])
    route_index = int(row["route_index"])

    route = candidate_routes[route_index]

    top5_instructions[rank] = generate_route_instructions(route)


# Display
for rank, instructions in top5_instructions.items():

    row = top_5_routes[
        top_5_routes["rank"] == rank
    ].iloc[0]

    print("=" * 70)
    print(
        f"RANK {rank} | "
        f"Route {int(row['route_index'])}"
    )

    print(
        f"Distance: {row['distance_km']:.3f} km | "
        f"Safety Score: {row['final_safety_score']:.2f}"
    )

    print("-" * 70)

    for instruction in instructions[:15]:

        print(
            f"{instruction['step']}. "
            f"Continue {instruction['direction']} "
            f"on {instruction['road']} "
            f"for {instruction['distance_m']:.0f} m"
        )

    if len(instructions) > 15:
        print(
            f"... {len(instructions) - 15} more steps"
        )

    print()

RANK 1 | Route 19
Distance: 5.572 km | Safety Score: 44.00
----------------------------------------------------------------------
1. Continue West on Unnamed road for 28 m
2. Continue South on Varasidhi Vinayakar Koil Street for 48 m
3. Continue South on Varasidhi Vinayakar Koil Street for 36 m
4. Continue South on Varasidhi Vinayakar Koil Street for 43 m
5. Continue South on Varasidhi Vinayakar Koil Street for 40 m
6. Continue South on Varasidhi Vinayakar Koil Street for 22 m
7. Continue East on EVR Periyar Salai for 84 m
8. Continue North-East on General Hospital Road for 8 m
9. Continue South on Raja Muthiah Road for 11 m
10. Continue South-West on EVR Periyar Salai for 9 m
11. Continue West on EVR Periyar Salai for 620 m
12. Continue South on Langs Garden Road for 225 m
13. Continue South on Gandhi Irwin Bridge Road for 6 m
14. Continue South on Gandhi Irwin Bridge Road for 232 m
15. Continue South on Gandhi Irwin Bridge Road for 10 m
... 77 more steps

RANK 2 | Route 9
Distance: 5

In [ ]:
def generate_clean_instructions(route):
    raw = generate_route_instructions(route)

    if not raw:
        return []

    merged = []

    for item in raw:

        if not merged:
            merged.append(item.copy())
            continue

        previous = merged[-1]

        # Merge consecutive segments on the same road
        if (
            item["road"] == previous["road"]
            and item["direction"] == previous["direction"]
        ):
            previous["distance_m"] += item["distance_m"]

        else:
            merged.append(item.copy())

    # Re-number instructions
    for i, item in enumerate(merged, start=1):
        item["step"] = i

    return merged


# Generate cleaned instructions for Top 5
top5_clean_instructions = {}

for _, row in top_5_routes.iterrows():

    rank = int(row["rank"])
    route_index = int(row["route_index"])

    route = candidate_routes[route_index]

    top5_clean_instructions[rank] = generate_clean_instructions(route)


# Display
for rank, instructions in top5_clean_instructions.items():

    row = top_5_routes[
        top_5_routes["rank"] == rank
    ].iloc[0]

    print("=" * 70)
    print(
        f"RANK {rank} | Route {int(row['route_index'])}"
    )

    print(
        f"Distance: {row['distance_km']:.3f} km | "
        f"Safety Score: {row['final_safety_score']:.2f}"
    )

    print("-" * 70)

    for instruction in instructions:

        print(
            f"{instruction['step']}. "
            f"Continue {instruction['direction']} "
            f"on {instruction['road']} "
            f"for {instruction['distance_m']:.0f} m"
        )

    print()

RANK 1 | Route 19
Distance: 5.572 km | Safety Score: 44.00
----------------------------------------------------------------------
1. Continue West on Unnamed road for 28 m
2. Continue South on Varasidhi Vinayakar Koil Street for 190 m
3. Continue East on EVR Periyar Salai for 84 m
4. Continue North-East on General Hospital Road for 8 m
5. Continue South on Raja Muthiah Road for 11 m
6. Continue South-West on EVR Periyar Salai for 9 m
7. Continue West on EVR Periyar Salai for 620 m
8. Continue South on Langs Garden Road for 225 m
9. Continue South on Gandhi Irwin Bridge Road for 248 m
10. Continue South-East on Unnamed road for 1 m
11. Continue South on Unnamed road for 12 m
12. Continue South-West on Unnamed road for 8 m
13. Continue South on Langs Garden Road for 194 m
14. Continue South-East on Langs Garden Road for 658 m
15. Continue South on Langs Garden Road for 133 m
16. Continue East on Harris Bridge for 97 m
17. Continue South on West Cooum River Road for 6 m
18. Continue East 

In [ ]:
def get_turn_direction(prev_bearing, current_bearing):
    """
    Convert bearing change into a navigation instruction.
    """
    diff = (current_bearing - prev_bearing + 180) % 360 - 180

    if abs(diff) < 20:
        return "Continue"

    if 20 <= diff < 60:
        return "Bear right"

    if 60 <= diff < 135:
        return "Turn right"

    if diff >= 135:
        return "Make a U-turn"

    if -60 < diff <= -20:
        return "Bear left"

    if -135 < diff <= -60:
        return "Turn left"

    return "Make a U-turn"


def generate_navigation_instructions(route):
    raw = generate_route_instructions(route)

    if not raw:
        return []

    # First merge consecutive segments with same road
    merged = []

    for item in raw:

        if not merged:
            merged.append(item.copy())
            continue

        previous = merged[-1]

        if item["road"] == previous["road"]:
            previous["distance_m"] += item["distance_m"]
            previous["latitude"] = item["latitude"]
            previous["longitude"] = item["longitude"]

        else:
            merged.append(item.copy())

    instructions = []

    previous_bearing = None

    for i, item in enumerate(merged):

        current_direction = item["direction"]

        # Convert compass direction to approximate bearing
        direction_bearing = {
            "North": 0,
            "North-East": 45,
            "East": 90,
            "South-East": 135,
            "South": 180,
            "South-West": 225,
            "West": 270,
            "North-West": 315
        }

        current_bearing = direction_bearing.get(
            current_direction,
            0
        )

        if i == 0:
            action = "Start"

        else:
            action = get_turn_direction(
                previous_bearing,
                current_bearing
            )

        instructions.append({
            "step": i + 1,
            "action": action,
            "road": item["road"],
            "distance_m": round(item["distance_m"], 1),
            "direction": current_direction,
            "latitude": item["latitude"],
            "longitude": item["longitude"]
        })

        previous_bearing = current_bearing

    # Final destination instruction
    if instructions:
        instructions.append({
            "step": len(instructions) + 1,
            "action": "Arrive",
            "road": "Marina Beach",
            "distance_m": 0,
            "direction": "",
            "latitude": instructions[-1]["latitude"],
            "longitude": instructions[-1]["longitude"]
        })

    return instructions


# Generate navigation instructions for Top 5
top5_navigation = {}

for _, row in top_5_routes.iterrows():

    rank = int(row["rank"])
    route_index = int(row["route_index"])

    top5_navigation[rank] = generate_navigation_instructions(
        candidate_routes[route_index]
    )


# Display
for rank, instructions in top5_navigation.items():

    row = top_5_routes[
        top_5_routes["rank"] == rank
    ].iloc[0]

    print("=" * 70)
    print(
        f"RANK {rank} | Route {int(row['route_index'])}"
    )

    print(
        f"Distance: {row['distance_km']:.3f} km | "
        f"Safety Score: {row['final_safety_score']:.2f}"
    )

    print("-" * 70)

    for instruction in instructions:

        if instruction["action"] == "Arrive":
            print(
                f"{instruction['step']}. "
                f"Arrive at {instruction['road']}"
            )
        else:
            print(
                f"{instruction['step']}. "
                f"{instruction['action']} "
                f"onto {instruction['road']} "
                f"for {instruction['distance_m']:.0f} m"
            )

    print()

RANK 1 | Route 19
Distance: 5.572 km | Safety Score: 44.00
----------------------------------------------------------------------
1. Start onto Unnamed road for 28 m
2. Turn left onto Varasidhi Vinayakar Koil Street for 190 m
3. Turn left onto EVR Periyar Salai for 84 m
4. Bear left onto General Hospital Road for 8 m
5. Make a U-turn onto Raja Muthiah Road for 11 m
6. Bear right onto EVR Periyar Salai for 628 m
7. Bear left onto Langs Garden Road for 225 m
8. Continue onto Gandhi Irwin Bridge Road for 248 m
9. Bear left onto Unnamed road for 22 m
10. Bear right onto Langs Garden Road for 985 m
11. Turn left onto Harris Bridge for 97 m
12. Turn right onto West Cooum River Road for 6 m
13. Turn left onto Unnamed road for 8 m
14. Continue onto Blackers Road for 198 m
15. Bear left onto Anna Salai (Mount Road) for 70 m
16. Turn right onto Unnamed road for 47 m
17. Continue onto Wallajah Road for 232 m
18. Turn right onto Triplicane High Road for 894 m
19. Make a U-turn onto Bharathi Salai 

In [ ]:
import folium
from branca.element import IFrame

# Create Chennai map
m = folium.Map(
    location=[13.0827, 80.2707],
    zoom_start=13,
    tiles="Esri.WorldStreetMap"
)

route_colors = [
    "red",
    "blue",
    "green",
    "purple",
    "orange"
]

for _, row in top_5_routes.iterrows():

    rank = int(row["rank"])
    route_index = int(row["route_index"])

    route = candidate_routes[route_index]

    route_coords = [
        (G.nodes[node]["y"], G.nodes[node]["x"])
        for node in route
    ]

    # Navigation instructions
    instructions = top5_navigation[rank]

    instruction_html = ""

    for instruction in instructions:

        if instruction["action"] == "Arrive":
            instruction_html += (
                f"<b>{instruction['step']}. "
                f"Arrive at {instruction['road']}</b><br>"
            )
        else:
            instruction_html += (
                f"{instruction['step']}. "
                f"{instruction['action']} "
                f"<b>{instruction['road']}</b> "
                f"({instruction['distance_m']:.0f} m)<br>"
            )

    popup_html = f"""
    <div style="width:350px; max-height:500px; overflow-y:auto;">

        <h3>SafeRoute - Rank {rank}</h3>

        <hr>

        <b>Route:</b> {route_index}<br>
        <b>Distance:</b> {row['distance_km']:.3f} km<br>
        <b>Safety Score:</b> {row['final_safety_score']:.2f}/100<br>
        <b>Base Risk:</b> {row['route_risk']:.2f}<br>
        <b>Live Traffic Risk:</b> {row['traffic_risk_100']:.2f}<br>
        <b>Road Closures:</b> {int(row['closure_segments'])}

        <hr>

        <h4>Turn-by-Turn Navigation</h4>

        {instruction_html}

    </div>
    """

    iframe = IFrame(
        popup_html,
        width=370,
        height=500
    )

    popup = folium.Popup(
        iframe,
        max_width=400
    )

    folium.PolyLine(
        route_coords,
        color=route_colors[rank - 1],
        weight=7,
        opacity=0.8,
        popup=popup,
        tooltip=(
            f"Rank {rank} | "
            f"Safety Score: {row['final_safety_score']:.2f}"
        )
    ).add_to(m)


# Start marker
folium.Marker(
    [13.0827, 80.2707],
    popup="<b>Start</b><br>Chennai Central",
    tooltip="Start",
    icon=folium.Icon(
        color="green",
        icon="play",
        prefix="fa"
    )
).add_to(m)


# Destination marker
folium.Marker(
    [13.0500, 80.2824],
    popup="<b>Destination</b><br>Marina Beach",
    tooltip="Destination",
    icon=folium.Icon(
        color="red",
        icon="flag",
        prefix="fa"
    )
).add_to(m)


display(m)

In [ ]:
import os
import joblib
import json

CHECKPOINT_DIR = "/content/saferoute_checkpoint"
os.makedirs(CHECKPOINT_DIR, exist_ok=True)

# --------------------------------------------------
# 1. ML MODEL
# --------------------------------------------------

joblib.dump(
    lgb_model_real_weather,
    f"{CHECKPOINT_DIR}/lightgbm_model.pkl"
)

with open(
    f"{CHECKPOINT_DIR}/ml_features.json",
    "w"
) as f:
    json.dump(ML_FEATURES, f)


# --------------------------------------------------
# 2. DATA / OSM OBJECTS
# --------------------------------------------------

objects_to_save = {
    "osm_ml": osm_ml,
    "candidate_routes": candidate_routes,
    "route_results_df": route_results_df,
    "route_traffic_summary": route_traffic_summary,
    "top_5_routes": top_5_routes,
    "weather_df": weather_df,
    "risk_lookup": risk_lookup,
    "top5_navigation": top5_navigation,
    "top5_clean_instructions": top5_clean_instructions,
}

joblib.dump(
    objects_to_save,
    f"{CHECKPOINT_DIR}/saferoute_objects.pkl"
)


# --------------------------------------------------
# 3. OSM GRAPH
# --------------------------------------------------

joblib.dump(
    G,
    f"{CHECKPOINT_DIR}/chennai_osm_graph.pkl"
)


# --------------------------------------------------
# 4. SAVE TOMTOM MATCH DATA IF AVAILABLE
# --------------------------------------------------

optional_objects = {
    "route_traffic_match": globals().get("route_traffic_match"),
    "route_traffic_clean": globals().get("route_traffic_clean"),
    "top5_navigation": globals().get("top5_navigation"),
}

joblib.dump(
    optional_objects,
    f"{CHECKPOINT_DIR}/traffic_navigation.pkl"
)


# --------------------------------------------------
# 5. SUMMARY
# --------------------------------------------------

print("SafeRoute checkpoint saved successfully.")
print(f"Location: {CHECKPOINT_DIR}")

print("\nSaved files:")

for file in sorted(os.listdir(CHECKPOINT_DIR)):
    size_mb = os.path.getsize(
        os.path.join(CHECKPOINT_DIR, file)
    ) / (1024 * 1024)

    print(f"  {file:<35} {size_mb:.2f} MB")

SafeRoute checkpoint saved successfully.
Location: /content/saferoute_checkpoint

Saved files:
  chennai_osm_graph.pkl               24.74 MB
  lightgbm_model.pkl                  3.00 MB
  ml_features.json                    0.00 MB
  saferoute_objects.pkl               93.05 MB
  traffic_navigation.pkl              0.57 MB


In [ ]:
import shutil

CHECKPOINT_ZIP = "/content/saferoute_checkpoint.zip"

shutil.make_archive(
    "/content/saferoute_checkpoint",
    "zip",
    CHECKPOINT_DIR
)

print(f"Created: {CHECKPOINT_ZIP}")

Created: /content/saferoute_checkpoint.zip


In [ ]:
from google.colab import files

files.download(
    "/content/saferoute_checkpoint.zip"
)

<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>

In [ ]:
# ============================================================
# TRAFFIC COVERAGE PER CANDIDATE ROUTE
# ============================================================

route_traffic_summary = (
    route_segments_with_traffic
    .groupby("route_index")
    .agg(
        total_segments=(
            "osm_segment_id",
            "count"
        ),
        traffic_observed=(
            "traffic_observed",
            "sum"
        ),
        closure_count=(
            "road_closure",
            lambda x: x.fillna(False).sum()
        ),
        mean_traffic_risk=(
            "traffic_risk_100",
            "mean"
        )
    )
    .reset_index()
)

route_traffic_summary["traffic_coverage_pct"] = (
    route_traffic_summary["traffic_observed"]
    / route_traffic_summary["total_segments"]
    * 100
)

display(route_traffic_summary)

KeyError: "Column(s) ['osm_segment_id'] do not exist"